# Dermoscopic lesion-classification benchmark — **runbook**

**Do not run this notebook top-to-bottom in one pass.** It has never been executed on a GPU. Run it
in stages and stop at each gate. The expensive stage is number 5; everything before it exists to
make sure you do not enter stage 5 with a broken pipeline.

| Stage | Cells | Time (EST.) | Gate — stop if this fails |
|---|---|---|---|
| **0** | 0.1–0.2 | instant | — |
| **1 Environment** | 2.1–2.5 | 5–10 min | GPU detected; all four dependency probes report their status |
| **2 Data** | 3.1–3.5 | 10–20 min | 10,015 HAM10000 images on disk; PH2 present *or* explicitly skipped |
| **3 Integrity** | 4.1–6.3 | 10–15 min | **every leakage-audit row PASS**; split fingerprint printed |
| **4 Models** | 7.1–7.4 + **Gate A** | 10–25 min | **highest dependency risk.** 4/4 models OK; drop-path identical; normalisation identical; DINOv3 token layout verified |
| **5a Calibration** | 8.1–9.2a + **Gate B** | 5–10 min | projected budget ≤ ceiling; no model dataloader-bound |
| **5b Smoke test** | 9.2b | 3–5 min | `run_experiment` completes on **both** protocol paths |
| **5c LR search** | 9.2c | 20–50 min | a learning rate selected for every model |
| **6 Benchmark** | 9.3 | 2–4 h | — |
| **7 Evaluation** | 10–17 | 30–60 min | — |
| **8 Ablation** | 18 | 30–60 min | disjoint control shows zero contamination (raises automatically) |
| **9 Export** | 19 | 2 min | — |

**Hard stop conditions.** Do not proceed past a stage if any of these fire — each means a result
would be wrong rather than merely disappointing:

- any leakage-audit row reports FAIL, including the transitive-closure check;
- the Vision-RWKV checkpoint tensor-match assertion fires (a mostly-random backbone would be
  benchmarked against three pretrained ones);
- the DINOv3 token-layout assertion fires (the wrong tokens would be averaged, and no downstream
  metric would reveal it);
- the label-mapping hash in Section 11 does not match the one frozen in Section 3.5;
- the corruption cache deviates from the reference pipeline;
- `[retrain] … checkpoint rejected` appears when you expected a clean resume.

**What to expect from the numbers.** Under a lesion-disjoint split, macro-F1 will land far below
the 95 %+ figures common in the HAM10000 literature. That is the protocol working as intended, not
underperformance — Section 18 measures the difference directly.

In [ ]:
# ============================================================================
# Cell 0.2 - Run control and stage gates
# ============================================================================
# Gates are asserts with an explanation attached. They exist because the failure modes
# in this pipeline are silent: a wrong register-token count, a stale checkpoint or a
# contaminated split all produce plausible numbers rather than an error.

STOP_ON_GATE_FAILURE = True      # False -> warn and continue (not recommended)
GATE_LOG: list[dict] = []

def gate(name: str, ok: bool, detail: str = "", advice: str = "") -> bool:
    """Record a stage gate; raise on failure unless explicitly overridden."""
    GATE_LOG.append({"gate": name, "passed": bool(ok), "detail": detail})
    mark = "PASS" if ok else "FAIL"
    print(f"  [{mark}] {name}" + (f"  -- {detail}" if detail else ""))
    if not ok:
        msg = f"GATE FAILED: {name}. {detail}"
        if advice:
            msg += f"\n  -> {advice}"
        if STOP_ON_GATE_FAILURE:
            raise RuntimeError(msg)
        print("  !! continuing despite failure (STOP_ON_GATE_FAILURE = False)")
    return bool(ok)

def gate_summary() -> None:
    if not GATE_LOG:
        print("No gates evaluated yet.")
        return
    import pandas as _pd            # 2.4 imports pandas; this keeps 0.2 standalone
    df = _pd.DataFrame(GATE_LOG)
    n_fail = int((~df.passed).sum())
    print("=" * 78)
    print(f"GATE SUMMARY - {len(df)} evaluated, {n_fail} failed")
    print("=" * 78)
    print(df.to_string(index=False))

print("Run control loaded.")
print(f"  STOP_ON_GATE_FAILURE = {STOP_ON_GATE_FAILURE}")
print("\nNext: Stage 1 (Section 2). Run one stage at a time and read each gate before")
print("continuing. `gate_summary()` prints every gate evaluated so far.")


Run control loaded.
  STOP_ON_GATE_FAILURE = True

Next: Stage 1 (Section 2). Run one stage at a time and read each gate before
continuing. `gate_summary()` prints every gate evaluated so far.


# Benchmarking Modern Vision Architectures for Dermoscopic Skin-Lesion Classification

**A reproducible, compute-budgeted comparison of a self-supervised Vision Foundation Model,
a modern CNN, a State-Space/Transformer hybrid, and a recurrent (RWKV-style) vision backbone.**

| | |
|---|---|
| **Primary dataset** | HAM10000 (~10,015 dermoscopic images, 7 diagnostic classes) |
| **External dataset** | BCN20000 (ISIC Archive, Hospital Clínic Barcelona; external validation only) |
| **Models** | DINOv3 ViT-S/16 · DeiT III ViT-S/16 · ConvNeXt V2-Tiny · Swin-T · ResNet-50 · EfficientNetV2-S · DenseNet-121 · MambaVision-T* · Vision-RWKV-T* (*excluded at the compatibility check) |
| **Target hardware** | Single NVIDIA L4 (Google Colab), no Google Drive |
| **Compute budget** | ~12-20 GPU-hours for the main experiment |
| **Target venue** | *Machine Vision and Applications* (Springer Nature) |

---

### Notebook contract

This notebook is written to be run **top-to-bottom on a fresh Colab L4 runtime**. It follows
three non-negotiable rules, in this priority order:

1. **Reproducibility** — every split, seed, hyperparameter, and measured runtime is recorded and
   exported. No number in any table is hard-coded or estimated by hand.
2. **Computational efficiency** — a two-stage transfer-learning schedule, mixed precision, and an
   automatically fitted batch size keep the study inside the stated budget.
3. **Visual polish** — last.

### What this notebook will *not* do

* It will not use Google Drive.
* It will not train any model from scratch.
* It will not silently substitute an architecture. If a model cannot be built, the
  **Compatibility Check** fails loudly, the model is *excluded*, and its exclusion is reported in
  every downstream table.
* It will not use the test set for model selection, and it will not claim that one model is better
  than another without a statistical test.
* It will not invent FLOPs, runtimes, p-values, or results. Anything that cannot be measured is
  reported as `N/A` with the reason.

---
## 1. Research Objective

### 1.1 Motivation

Automated dermoscopic lesion classification is dominated by ImageNet-pretrained CNNs and, more
recently, by supervised Vision Transformers. Three developments make a fresh architectural
comparison timely:

1. **Self-supervised vision foundation models** (DINOv3) now provide dense, general-purpose visual
   features learned without labels, and are reported to transfer strongly to specialised domains.
2. **Modern CNNs** (ConvNeXt V2, pretrained with a fully convolutional masked autoencoder) remain
   highly competitive while retaining the inductive biases that suit texture-dominated imagery.
3. **Sub-quadratic sequence backbones** — State-Space Models (MambaVision) and linear-attention /
   recurrent formulations (Vision-RWKV) — promise Transformer-level accuracy at lower asymptotic
   cost, but have been evaluated almost exclusively on natural-image benchmarks.

### 1.2 Research questions

* **RQ1** — Under an identical data pipeline, split, budget, and training schedule, do the four
  architecture families differ *significantly* on 7-class HAM10000 classification?
* **RQ2** — Does the ranking obtained on HAM10000 survive an **external** evaluation on PH2, i.e.
  under acquisition-related domain shift?
* **RQ3** — How do the architectures degrade under common photometric and sensor corruptions
  applied at test time only?
* **RQ4** — What is the accuracy-versus-cost trade-off in measured parameters, FLOPs, latency,
  throughput, and training time?

### 1.3 Experimental design summary

* **Experiment A** — 7-class classification on HAM10000, lesion-disjoint 70/15/15 split,
  5 seeds (42, 123, 2024, 7, 2718) per model.
* **Experiment B** — Cross-dataset binary evaluation (melanoma vs. nevus) on PH2, using the
  HAM10000-trained weights **without any retraining or fine-tuning**, through a label mapping that
  is defined and printed *before* PH2 is ever touched.
* **Experiment C** — Corruption robustness, applied on-the-fly to the held-out test data.
* **Experiment D** — Measured computational efficiency.

Statistical inference uses **McNemar's test** on paired test-set predictions with **Holm**
correction across the six model pairs, plus mean / SD / 95% CI across seeds.

### 1.1 What this study is, and what it is not

Two framing decisions govern everything below, and both are constraints rather than choices.

**This is not an architecture comparison.** The four backbones were pretrained on corpora that
differ by roughly three orders of magnitude — DINOv3 on ~1.7 billion images with a self-supervised
objective, ConvNeXt V2 on ImageNet-22k, MambaVision and Vision-RWKV on ImageNet-1k with supervised
objectives. Architecture is therefore fully confounded with pretraining data, scale and objective,
and no analysis of these results can separate them. Isolating architecture would require
pretraining all four backbones on one identical corpus, which is thousands of GPU-hours out of
scope. The defensible claim is about **publicly available pretrained configurations under a
controlled, equal fixed transfer budget** — which is the question a practitioner choosing a
backbone actually faces. Section 18's frozen-versus-fine-tuned contrast is the only affordable
instrument that partially decomposes the confound, and every performance table carries the
pretraining corpus and scale alongside the numbers so the confound stays visible.

**The evaluation protocol is a first-class object of study, not a preliminary.** HAM10000 contains
multiple photographs of the same physical lesion, so an image-level random split places different
views of one lesion on both sides of the partition. Published results on this dataset frequently
exceed 95 % accuracy under such splits. Section 18 measures what that protocol choice is worth, in
this specific setting, using the same four models and the same hyperparameters — changing only the
split. The question it answers is not merely whether numbers inflate, but whether the inflation is
uniform across architecture families: if it is not, the evaluation protocol can reorder
conclusions rather than merely shift them.

### 1.2 Coverage

Three of the four families are already represented in the dermoscopy literature — modern CNNs,
Vision Transformers, and more recently Mamba/SSM hybrids. Linear-recurrent (RWKV-style) vision
backbones are not, which is why Vision-RWKV-T is included and why the notebook refuses to
substitute it if its pretrained weights cannot be verified.


---
## 2. Environment Setup

### 2.1 Hardware and runtime probe

Run this first. If no GPU is reported, set **Runtime → Change runtime type → GPU (L4)** and
re-run. The notebook is *functional* on other GPUs (T4, A100), but the compute-budget figures in
Section 16 are only comparable to the manuscript when an L4 is used.

In [ ]:
# ============================================================================
# Cell 2.1 - Hardware / runtime probe
# ============================================================================
import subprocess, sys, platform, os

print("=" * 78)
print("RUNTIME PROBE")
print("=" * 78)
print(f"Python           : {sys.version.split()[0]}  ({platform.platform()})")

try:
    smi = subprocess.run(["nvidia-smi"], capture_output=True, text=True, timeout=60)
    print(smi.stdout if smi.returncode == 0 else "nvidia-smi failed:\n" + smi.stderr)
except Exception as e:  # noqa: BLE001
    print(f"nvidia-smi unavailable: {e}")

try:
    import torch
    print(f"PyTorch          : {torch.__version__}")
    print(f"CUDA (torch)     : {torch.version.cuda}")
    print(f"cuDNN            : {torch.backends.cudnn.version()}")
    print(f"CUDA available   : {torch.cuda.is_available()}")
    if torch.cuda.is_available():
        p = torch.cuda.get_device_properties(0)
        print(f"GPU              : {p.name}")
        print(f"GPU memory       : {p.total_memory / 1024**3:.1f} GiB")
        print(f"Compute cap.     : {p.major}.{p.minor}")
        print(f"bfloat16 support : {torch.cuda.is_bf16_supported()}")
    else:
        print("\n*** NO GPU DETECTED - switch the Colab runtime to GPU before continuing. ***")
except ImportError:
    print("PyTorch not importable yet; it will be installed in the next cell.")

try:
    nvcc = subprocess.run(["nvcc", "--version"], capture_output=True, text=True, timeout=60)
    print("\nnvcc:\n" + (nvcc.stdout.strip() if nvcc.returncode == 0 else "not found"))
except Exception:  # noqa: BLE001
    print("\nnvcc: not found (needed only for the Vision-RWKV custom CUDA op)")
print("=" * 78)

RUNTIME PROBE
Python           : 3.13.15  (Linux-6.6.122+-x86_64-with-glibc2.35)
Sat Aug 29 00:44:05 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 580.82.07              Driver Version: 580.82.07      CUDA Version: 13.0     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  NVIDIA L4                      Off |   00000000:00:03.0 Off |                    0 |
| N/A   31C    P8             12W /   72W |       0MiB /  23034MiB |      0%      Default |
|                                         |                

### 2.2 Core package installation

Only packages that are actually used are installed. Colab already ships a working
PyTorch + CUDA stack, so **PyTorch is deliberately not reinstalled** — reinstalling it is the
single most common cause of broken Colab runtimes.

| Package | Purpose |
|---|---|
| `timm` | ConvNeXt V2-Tiny weights, transform configs, layer utilities |
| `transformers`, `huggingface_hub` | DINOv3 and MambaVision official checkpoints |
| `einops` | required by MambaVision / Vision-RWKV source |
| `scikit-learn` | grouped stratified splitting, metrics, ROC |
| `statsmodels` | McNemar's test, Holm correction |
| `fvcore` | FLOP counting (reported as `N/A` where operators are unsupported) |
| `kagglehub` | optional HAM10000 mirror if Harvard Dataverse is unreachable |

In [ ]:
# ============================================================================
# Cell 2.2 - Core packages
# ============================================================================
# Colab ships torch, torchvision, Pillow and NumPy as a MATCHED, COMPILED set.
# Moving any one of them breaks the others, and each break costs a whole runtime:
#
#   pillow upgraded under torchvision -> ImportError: cannot import name '_Ink'
#                                        from 'PIL._typing'
#   torchvision changed under torch   -> RuntimeError: operator torchvision::nms
#                                        does not exist
#
# So the versions already present are read and passed to pip as hard pins. If some
# other requirement wants a different Pillow, pip now reports a conflict instead of
# silently rearranging the runtime. `--upgrade` is deliberately NOT used: with
# lower-bound requirements pip already upgrades only what fails the bound.

import sys, subprocess, importlib

def _pin(mod: str, pkg: str = "") -> str:
    try:
        return f"{pkg or mod}=={importlib.import_module(mod).__version__}"
    except Exception:  # noqa: BLE001
        return ""

GUARD_PINS = [p for p in (_pin("PIL", "pillow"), _pin("numpy")) if p]

REQS = ["timm>=1.0.11", "transformers>=4.56.0", "huggingface_hub>=0.34.0", "einops",
        "scikit-learn>=1.4", "statsmodels>=0.14", "fvcore", "kagglehub",
        "pandas>=2.0,<3", "matplotlib", "tqdm", "openpyxl"]

print("Protecting the preinstalled compiled set:")
print("  " + (", ".join(GUARD_PINS) if GUARD_PINS else "(none detected)"))
_r = subprocess.run([sys.executable, "-m", "pip", "install", "-q", *REQS, *GUARD_PINS],
                    capture_output=True, text=True)
if _r.returncode != 0:
    print("\npip reported a problem:\n" + "\n".join(_r.stderr.strip().splitlines()[-12:]))
    print("\nIf the conflict names pillow or numpy, a requirement above wants a version")
    print("that would break torchvision. Relax that requirement rather than the pin.")

# ---- verify the compiled set still imports, in a SUBPROCESS ------------------
# A subprocess tests the on-disk state without contaminating this kernel, and it
# fails here rather than four cells later with a misleading message.
_probe = subprocess.run(
    [sys.executable, "-c",
     "import torch, torchvision, PIL, numpy, pandas;"
     "print(torch.__version__, torchvision.__version__, PIL.__version__,"
     " numpy.__version__, pandas.__version__)"],
    capture_output=True, text=True)
if _probe.returncode == 0:
    _t, _tv, _pil, _np, _pd = _probe.stdout.split()
    print("\nCompiled set intact:")
    print(f"  torch {_t} | torchvision {_tv} | Pillow {_pil} | numpy {_np} | pandas {_pd}")
else:
    print("\n" + "=" * 78)
    print("THE COMPILED SET IS BROKEN. Do not continue - later cells will fail with")
    print("confusing errors far from the real cause. The probe reported:")
    print("=" * 78)
    print(_probe.stderr.strip().splitlines()[-1] if _probe.stderr.strip() else "unknown")
    print("=" * 78)
    print("Recover with: Runtime -> Disconnect and delete runtime, then re-run from")
    print("Cell 0.2. Do NOT pip-install torch, torchvision or pillow to patch it -")
    print("that is what breaks the runtime in the first place.")
    raise RuntimeError("torch / torchvision / Pillow are mutually inconsistent "
                       "on disk - delete the runtime and start again.")


Protecting the preinstalled compiled set:
  pillow==11.3.0, numpy==2.1.3

Compiled set intact:
  torch 2.11.0+cu128 | torchvision 0.26.0+cu128 | Pillow 11.3.0 | numpy 2.1.3 | pandas 2.2.3


### 2.3 Optional heavy dependencies (MambaVision, Vision-RWKV)

Two of the four architectures need dependencies that are *not* pure Python:

* **MambaVision-T** uses NVIDIA's official implementation, whose selective-scan mixer imports
  `mamba_ssm` (and optionally `causal_conv1d`). Both are CUDA extensions. Building them from
  source on Colab takes 20-40 minutes, so this cell first tries the **official prebuilt wheels**
  published by the upstream repositories, matched against the detected Python / PyTorch / CUDA
  ABI, and only falls back to a source build if you opt in.
* **Vision-RWKV-T** uses OpenGVLab's official backbone, which JIT-compiles a custom bidirectional
  WKV CUDA kernel with `torch.utils.cpp_extension`. That compilation happens later, at model build
  time, and needs `nvcc` (present on Colab).

**If a dependency cannot be installed, nothing is silently replaced.** The Compatibility Check in
Section 7.5 will mark the affected model as `FAILED`, print the exact exception, and exclude it
from the benchmark.

In [ ]:
# ============================================================================
# Cell 2.3 - Optional CUDA-extension dependencies (MambaVision, Vision-RWKV)
# ============================================================================
# Wheel URLs are DISCOVERED from the GitHub releases API rather than hard-coded.
# Hard-coded tags go stale silently: a 404 looks like "no wheel for your platform"
# when the real cause is that the pinned release was superseded months ago.

ALLOW_MAMBA_SOURCE_BUILD = False   # True -> permit a 20-40 min source build

# torch.utils.cpp_extension.load() shells out to ninja, and Colab images do not always
# ship it. Without it Vision-RWKV fails with 'Ninja is required to load C++ extensions'
# before any of its own code runs - which looks like an architecture problem and is not.
import subprocess as _sp, sys as _sys
_sp.run([_sys.executable, "-m", "pip", "install", "-q", "ninja"], capture_output=True)
_nj = _sp.run(["ninja", "--version"], capture_output=True, text=True)
print(f"ninja: {_nj.stdout.strip() if _nj.returncode == 0 else 'NOT AVAILABLE'}"
      + ("" if _nj.returncode == 0 else
         "  <- Vision-RWKV cannot JIT-compile its CUDA kernel without this"))

import sys, subprocess, importlib, json as _json, urllib.request, re, platform, torch

def _pip(*args) -> bool:
    r = subprocess.run([sys.executable, "-m", "pip", "install", "-q", *args],
                       capture_output=True, text=True)
    if r.returncode != 0:
        tail = r.stderr.strip().splitlines()
        print("    pip failed:", tail[-1] if tail else "unknown")
    return r.returncode == 0

def _have(mod: str) -> bool:
    try:
        importlib.import_module(mod)
        return True
    except Exception:  # noqa: BLE001
        return False

PY_TAG = f"cp{sys.version_info.major}{sys.version_info.minor}"
TORCH_V = torch.__version__.split("+")[0]
TORCH_MM = ".".join(TORCH_V.split(".")[:2])
CU_MAJOR = "cu" + (torch.version.cuda or "12.0").split(".")[0]
# These repos publish BOTH x86_64 and aarch64 wheels. Colab is x86_64; an aarch64
# wheel installs nothing useful and only wastes a pip round-trip.
ARCH_TAG = f"linux_{platform.machine()}"
print("=" * 78)
print(f"Target ABI: python {PY_TAG} | torch {TORCH_MM} | {CU_MAJOR} | {ARCH_TAG}")
print("=" * 78)

def _releases(repo: str, n: int = 8) -> list:
    try:
        req = urllib.request.Request(
            f"https://api.github.com/repos/{repo}/releases?per_page={n}",
            headers={"Accept": "application/vnd.github+json", "User-Agent": "benchmark"})
        return _json.load(urllib.request.urlopen(req, timeout=30))
    except Exception as e:  # noqa: BLE001
        print(f"    could not query {repo} releases ({type(e).__name__}); "
              "falling back to source build only")
        return []

def _find_wheels(repo: str) -> tuple[list, set]:
    """Return (matching wheel URLs, torch versions that DO have wheels)."""
    urls, torch_seen = [], set()
    for rel in _releases(repo):
        for a in rel.get("assets", []):
            name = a["name"]
            if not name.endswith(".whl"):
                continue
            m = re.search(r"torch(\d+\.\d+)", name)
            if m:
                torch_seen.add(m.group(1))
            if (m and m.group(1) == TORCH_MM and PY_TAG in name
                    and CU_MAJOR in name and ARCH_TAG in name):
                urls.append(a["browser_download_url"])
        if urls:                      # newest release that matches wins
            break
    # try the ABI the interpreter actually uses first
    abi = "TRUE" if torch._C._GLIBCXX_USE_CXX11_ABI else "FALSE"
    urls.sort(key=lambda u: 0 if f"cxx11abi{abi}" in u else 1)
    return urls, torch_seen

def try_install(repo: str, module: str, label: str) -> bool:
    print(f"\n[{label}]")
    if _have(module):
        print("    already importable")
        return True
    urls, torch_seen = _find_wheels(repo)
    for u in urls:
        print(f"    trying {u.rsplit('/', 1)[-1]}")
        if _pip(u) and _have(module):
            print("    -> installed")
            return True
    if not urls:
        avail = ", ".join(sorted((v for v in torch_seen if v[0] == "2"),
                                 key=lambda s: [int(x) for x in s.split(".")]))
        print(f"    no prebuilt wheel for torch {TORCH_MM} / {PY_TAG} / {CU_MAJOR} / {ARCH_TAG}")
        if avail:
            print(f"    wheels DO exist for torch: {avail}")
            print(f"    -> this runtime's torch ({TORCH_V}) is newer than anything "
                  f"{label} has published")
    return False

CONV1D_OK = try_install("Dao-AILab/causal-conv1d", "causal_conv1d",
                        "causal_conv1d (optional speed-up for mamba_ssm)")
MAMBA_OK = try_install("state-spaces/mamba", "mamba_ssm",
                       "mamba_ssm (REQUIRED by the official MambaVision mixer)")

if not MAMBA_OK and ALLOW_MAMBA_SOURCE_BUILD:
    print("\n[source build] compiling mamba_ssm - this takes 20-40 minutes")
    _pip("--no-build-isolation", "mamba-ssm")
    MAMBA_OK = _have("mamba_ssm")

if MAMBA_OK:
    _pip("mambavision")
    print("\nmamba_ssm available - MambaVision-T will be included.")
else:
    print("\n" + "=" * 78)
    print("mamba_ssm NOT available.")
    print("  MambaVision-T will be reported FAILED in Gate A and EXCLUDED from the")
    print("  benchmark. It will NOT be replaced by a different architecture, and every")
    print("  table will show it as EXCLUDED with this exact reason.")
    print("")
    print("  Your options, in order of cost:")
    print("   (a) Proceed with three architectures. Defensible, but say so explicitly")
    print("       and drop the SSM/hybrid family from the scope statement.")
    print("   (b) Set ALLOW_MAMBA_SOURCE_BUILD = True and re-run this cell (20-40 min,")
    print("       and it may still fail if the package has not caught up to this torch).")
    print("   (c) Use a runtime whose torch version has published wheels (see the list")
    print("       printed above). Do NOT pip-install a different torch into this")
    print("       runtime - that breaks torchvision and the whole session with it.")
    print("=" * 78)


ninja: 1.13.0.git.kitware.jobserver-pipe-1
Target ABI: python cp313 | torch 2.11 | cu12 | linux_x86_64

[causal_conv1d (optional speed-up for mamba_ssm)]
    no prebuilt wheel for torch 2.11 / cp313 / cu12 / linux_x86_64
    wheels DO exist for torch: 2.6, 2.7, 2.8, 2.9, 2.10, 25.09, 25.10, 25.11, 25.12, 26.01, 26.02, 26.03, 26.04, 26.05, 26.06, 26.07
    -> this runtime's torch (2.11.0) is newer than anything causal_conv1d (optional speed-up for mamba_ssm) has published

[mamba_ssm (REQUIRED by the official MambaVision mixer)]
    no prebuilt wheel for torch 2.11 / cp313 / cu12 / linux_x86_64
    wheels DO exist for torch: 2.4, 2.5, 2.6, 2.7, 2.8, 2.9, 2.10, 24.01, 25.04, 25.05, 25.06, 25.08, 25.09, 25.10, 25.11, 25.12, 26.01, 26.02, 26.03, 26.04
    -> this runtime's torch (2.11.0) is newer than anything mamba_ssm (REQUIRED by the official MambaVision mixer) has published

mamba_ssm NOT available.
  MambaVision-T will be reported FAILED in Gate A and EXCLUDED from the
  benchmark. It

### 2.4 Imports, deterministic seeding, and timing infrastructure

**On determinism.** We fix the Python, NumPy, PyTorch, and CUDA seeds, and we use a *fixed*
dataset split shared by every model and every seed (this is what makes the paired McNemar test
valid). We deliberately do **not** enable `torch.use_deterministic_algorithms(True)` by default:
several operators in the SSM and RWKV backbones have no deterministic CUDA implementation, and
forcing determinism where it does exist costs roughly 15-30 % throughput. Bit-exact
reproducibility is therefore *not* claimed; instead, run-to-run variability is **measured and
reported** as the seed-level SD and 95 % CI in Section 10. Set `DETERMINISTIC = True` below to
trade speed for stricter reproducibility.

In [ ]:
# ============================================================================
# Cell 2.4 - Imports, seeding, timing
# ============================================================================
import os, sys, json, time, math, random, hashlib, shutil, zipfile, warnings, io, re, gc, types, contextlib
from pathlib import Path
from dataclasses import dataclass, asdict
from collections import OrderedDict
from concurrent.futures import ThreadPoolExecutor
from datetime import datetime, timezone

import numpy as np
import pandas as pd
import torch
import torch.nn as nn
import torch.nn.functional as F
from torch.utils.data import Dataset, DataLoader
# --- compiled-set consistency check (diagnose, never auto-install) -----------
# torchvision has a compiled extension bound to one torch ABI, and it also imports
# private Pillow internals. Either can break it, and the two need different fixes,
# so the failure is attributed rather than lumped together.
_tmaj, _tmin = (int(x) for x in torch.__version__.split("+")[0].split(".")[:2])
_expected_tv = f"0.{_tmin + 15}" if _tmaj == 2 else "?"
try:
    import torchvision
    _tv = torchvision.__version__.split("+")[0]
    import PIL
    if _expected_tv != "?" and not _tv.startswith(_expected_tv):
        raise RuntimeError(f"torch {torch.__version__} expects torchvision "
                           f"{_expected_tv}.x, found {_tv}")
    print(f"torch {torch.__version__} | torchvision {torchvision.__version__} | "
          f"Pillow {PIL.__version__}  [consistent]")
except ImportError as _e:
    _msg = str(_e)
    if "PIL" in _msg or "Pillow" in _msg:
        raise RuntimeError(
            f"Pillow is incompatible with the installed torchvision: {_msg}\n\n"
            "  This is a PILLOW fault, not a torch fault - torchvision imports private\n"
            "  Pillow internals that move between Pillow major versions. Something\n"
            "  upgraded Pillow away from the version Colab shipped.\n\n"
            "  Fix: Runtime -> Disconnect and delete runtime, then re-run from Cell 0.2.\n"
            "  Cell 2.2 pins Pillow to the preinstalled version so this cannot recur.\n"
            "  Do NOT install a torchvision version to work around it - that replaces\n"
            "  torch as well and produces a second, harder failure.") from _e
    raise RuntimeError(
        f"torchvision could not be imported: {_msg}\n\n"
        f"  torch {torch.__version__} pairs with torchvision {_expected_tv}.x.\n"
        "  Recover with: Runtime -> Disconnect and delete runtime.") from _e
except RuntimeError as _e:
    raise RuntimeError(
        f"torch/torchvision ABI mismatch: {_e}\n\n"
        "  DO NOT pip-install a torchvision version to 'fix' this: pip pulls its own\n"
        "  torch in behind it, and the torch already imported in this kernel will no\n"
        "  longer match the compiled extension.\n\n"
        "  Recover with: Runtime -> Disconnect and delete runtime, then re-run from\n"
        "  Cell 0.2. That restores Colab's matched pair.") from _e

import torchvision.transforms as T
from PIL import Image, ImageFilter

import matplotlib
matplotlib.use("Agg")
import matplotlib.pyplot as plt

from sklearn.model_selection import StratifiedGroupKFold
from sklearn.metrics import (accuracy_score, balanced_accuracy_score, precision_score,
                             recall_score, f1_score, confusion_matrix, roc_auc_score,
                             roc_curve)
from statsmodels.stats.contingency_tables import mcnemar
from statsmodels.stats.multitest import multipletests
from tqdm.auto import tqdm

warnings.filterwarnings("ignore", category=UserWarning)
warnings.filterwarnings("ignore", category=FutureWarning)
Image.MAX_IMAGE_PIXELS = None

DETERMINISTIC = False   # see the note above

def set_all_seeds(seed: int) -> None:
    """Seed every RNG that can influence a training run."""
    os.environ["PYTHONHASHSEED"] = str(seed)
    random.seed(seed)
    np.random.seed(seed)
    torch.manual_seed(seed)
    torch.cuda.manual_seed(seed)
    torch.cuda.manual_seed_all(seed)
    if DETERMINISTIC:
        torch.backends.cudnn.deterministic = True
        torch.backends.cudnn.benchmark = False
        os.environ["CUBLAS_WORKSPACE_CONFIG"] = ":4096:8"
        try:
            torch.use_deterministic_algorithms(True, warn_only=True)
        except Exception as e:  # noqa: BLE001
            print(f"[seed] deterministic algorithms not fully available: {e}")
    else:
        torch.backends.cudnn.deterministic = False
        torch.backends.cudnn.benchmark = True

def seed_worker(worker_id: int) -> None:
    """DataLoader worker seeding (worker RNGs are otherwise process-dependent)."""
    worker_seed = torch.initial_seed() % 2**32
    np.random.seed(worker_seed)
    random.seed(worker_seed)

# ---------------------------------------------------------------- timing ----
class Timer:
    """Context manager that records wall-clock seconds into the global TIMINGS registry."""
    def __init__(self, name: str, store: dict | None = None, verbose: bool = True):
        self.name, self.store, self.verbose = name, store, verbose
    def __enter__(self):
        if torch.cuda.is_available():
            torch.cuda.synchronize()
        self.t0 = time.perf_counter()
        return self
    def __exit__(self, *exc):
        if torch.cuda.is_available():
            torch.cuda.synchronize()
        self.elapsed = time.perf_counter() - self.t0
        if self.store is not None:
            self.store[self.name] = self.store.get(self.name, 0.0) + self.elapsed
        if self.verbose:
            print(f"[timer] {self.name}: {self.elapsed:.2f} s")
        return False

TIMINGS: dict[str, float] = {}
NOTEBOOK_T0 = time.perf_counter()

def fmt_hms(seconds: float) -> str:
    seconds = float(max(seconds, 0.0))
    h, rem = divmod(int(round(seconds)), 3600)
    m, s = divmod(rem, 60)
    return f"{h:d}h {m:02d}m {s:02d}s"

DEVICE = torch.device("cuda" if torch.cuda.is_available() else "cpu")
GPU_NAME = torch.cuda.get_device_name(0) if torch.cuda.is_available() else "CPU-only"
print(f"Device: {DEVICE}  ({GPU_NAME})")
print(f"Versions -> torch {torch.__version__} | numpy {np.__version__} | pandas {pd.__version__}")
import sklearn, timm, transformers
print(f"            sklearn {sklearn.__version__} | timm {timm.__version__} | "
      f"transformers {transformers.__version__}")

torch 2.11.0+cu128 | torchvision 0.26.0+cu128 | Pillow 11.3.0  [consistent]
Device: cuda  (NVIDIA L4)
Versions -> torch 2.11.0+cu128 | numpy 2.1.3 | pandas 2.2.3
            sklearn 1.6.1 | timm 1.0.28 | transformers 5.15.1


### 2.5 Global configuration

Every hyperparameter used anywhere in the notebook lives in this single object, is exported to
`config.json`, and is reproduced verbatim in **Table 2**. Justifications for each choice are given
in Section 8.

In [ ]:
# ============================================================================
# Cell 2.5 - Global configuration
# ============================================================================
@dataclass
class Config:
    # --- experiment identity -------------------------------------------------
    experiment_name: str = "mva_dermoscopy_benchmark_v1"
    # Two independent runs put the two models 0.012-0.013 macro-F1 apart with a mean
    # seed SD of 0.010-0.013, and the paired bootstrap found no significant difference in
    # 0/n seeds both times. Seed noise is the same size as the effect being measured, so
    # the CI is the binding constraint. n=3 -> n=5 takes t/sqrt(n) from 2.484 to 1.242,
    # which halves every confidence interval for 1.67x the training cost.
    seeds: tuple = (42, 123, 2024, 7, 2718)          # 5 seeds; do NOT extend without re-budgeting compute
    split_seed: int = 20240101              # split seed is FIXED and independent of model seeds

    # --- data ----------------------------------------------------------------
    img_size: int = 224
    train_frac: float = 0.70
    val_frac: float = 0.15
    test_frac: float = 0.15
    cache_resized: bool = True              # pre-resize images once -> large dataloading speed-up
    # Exact byte-duplicates are retained by default: they sit inside a single lesion,
    # the lesion-disjoint split keeps them in one partition, and keeping them preserves
    # the canonical 10,015-image count that the literature reports. Set True for a
    # sensitivity check - the split fingerprint and all totals will change.
    drop_exact_duplicates: bool = False
    cache_short_side: int = 256
    num_workers: int = -1                   # -1 -> auto-detect. Dataloading, not the GPU,
                                            #   is the usual bottleneck on Colab: see 8.4.
    prefetch_factor: int = 6

    # --- optimisation --------------------------------------------------------
    stage1_epochs: int = 4                  # frozen backbone, head only
    # Every run in v12 used its full budget with early_stopped=False and best_epoch in
    # {12, 13}: training was still improving when it was cut off. Any ranking measured
    # there is a ranking of under-trained models. Patience (3) still governs the actual
    # stopping point, so a model that converges early costs nothing extra.
    stage2_epochs: int = 16                 # full fine-tuning  -> 20 epochs total
    early_stopping_patience: int = 3        # on validation macro-F1, stage 2 only
    early_stopping_min_delta: float = 1e-4
    lr_head_stage1: float = 1e-3
    lr_head_stage2: float = 1e-4
    # RETIRED in v2 - kept only so old configs still load. These two fields assigned a
    # learning rate by architecture family, which confounded architecture with LR in the
    # headline comparison. Section 9.2c selects the backbone LR per model on validation.
    lr_backbone_vit: float = 1e-5
    lr_backbone_conv: float = 5e-5
    weight_decay: float = 1e-4
    warmup_frac: float = 0.1                # fraction of stage-2 steps used for linear warm-up
    grad_clip: float = 1.0
    drop_path_rate: float = 0.0             # stochastic depth. Applied identically to every
                                            #   backbone that exposes it. v1 gave Vision-RWKV
                                            #   0.1 and the other three 0.0, which is an
                                            #   uncontrolled regularisation difference.
    label_smoothing: float = 0.0            # kept at 0: interacts with class weighting
    max_batch_size: int = 64
    min_batch_size: int = 8
    amp: bool = True

    # --- fairness: backbone LR chosen per model on VALIDATION ---------------
    # A single hard-coded LR per *family* confounds architecture with learning
    # rate. Each model instead gets an identical search budget and the winner is
    # selected on validation macro-F1 (never on test).
    lr_search: bool = True
    # v12's grid (1e-5, 3e-5, 1e-4) was selected at its MAXIMUM by both models, with
    # validation macro-F1 still rising at the edge. A search that terminates on its own
    # boundary has not found an optimum, so the grid is extended upward. 1e-5 is dropped
    # because it lost decisively for both models (0.581 and 0.590).
    lr_grid: tuple = (3e-5, 1e-4, 3e-4, 1e-3)
    lr_search_epochs: int = 3                # stage-2 epochs per (model, LR) probe
    lr_search_seed: int = 42
    lr_backbone_default: float = 3e-5        # used only if lr_search is disabled

    # --- evaluation ----------------------------------------------------------
    ci_level: float = 0.95
    robustness_seeds: tuple = (42, 123, 2024)
    mcnemar_exact_threshold: int = 25       # exact binomial when b + c < 25

    # --- paths (all under /content - NO Google Drive) ------------------------
    root: str = "/content"
    def __post_init__(self):
        r = Path(self.root)
        self.data_dir = r / "data"
        self.ham_dir = self.data_dir / "HAM10000"
        self.ext_dir = self.data_dir / "external"
        self.ckpt_dir = r / "checkpoints"
        self.out_dir = r / "results"
        self.fig_dir = self.out_dir / "figures"
        self.tab_dir = self.out_dir / "tables"
        self.pred_dir = self.out_dir / "predictions"
        for d in (self.data_dir, self.ham_dir, self.ext_dir, self.ckpt_dir,
                  self.out_dir, self.fig_dir, self.tab_dir, self.pred_dir):
            d.mkdir(parents=True, exist_ok=True)

    @property
    def total_epochs(self) -> int:
        return self.stage1_epochs + self.stage2_epochs

CFG = Config()

# ---- dataloader workers ----------------------------------------------------
# Colab L4 runtimes are g2-standard-* machines with 8-12 vCPUs. The dermoscopy
# augmentation pipeline (RandomResizedCrop + rotation + ColorJitter, all PIL) costs
# far more CPU than the backbone costs GPU, so too few workers leaves the GPU idle
# while the Colab meter runs. Section 8.4 measures whether this is still binding.
if CFG.num_workers < 0:
    CFG.num_workers = max(2, min(8, (os.cpu_count() or 4) - 1))
print(f"Dataloader workers : {CFG.num_workers}  (os.cpu_count() = {os.cpu_count()})")

# ---- mixed precision (defined here so the compatibility check in 7.4 uses the
#      *same* dtype the training loop will use) ------------------------------
CFG.amp = CFG.amp and torch.cuda.is_available()
AMP_DTYPE = (torch.bfloat16 if (torch.cuda.is_available() and torch.cuda.is_bf16_supported())
             else torch.float16)
USE_SCALER = CFG.amp and AMP_DTYPE == torch.float16
print(f"Mixed precision    : {'enabled' if CFG.amp else 'disabled'} | dtype={AMP_DTYPE} "
      f"| GradScaler={'yes' if USE_SCALER else 'no (bf16 needs none)'}")

# ---- HAM10000 label space (fixed order, used everywhere) --------------------
CLASSES = ["akiec", "bcc", "bkl", "df", "mel", "nv", "vasc"]
CLASS_LONG = {
    "akiec": "Actinic keratosis / intraepithelial carcinoma",
    "bcc":   "Basal cell carcinoma",
    "bkl":   "Benign keratosis-like lesion",
    "df":    "Dermatofibroma",
    "mel":   "Melanoma",
    "nv":    "Melanocytic nevus",
    "vasc":  "Vascular lesion",
}
CLASS_TO_IDX = {c: i for i, c in enumerate(CLASSES)}
# Corruption names are declared here (used by the budget projection in 9.2a); the
# transforms themselves are defined in Section 13.
CORRUPTION_NAMES = ["brightness_0.7", "brightness_1.3", "contrast_0.7", "contrast_1.3",
                    "gauss_noise_005", "gauss_noise_010", "gauss_blur_1.0", "gauss_blur_2.0",
                    "jpeg_q50", "jpeg_q30"]
NUM_CLASSES = len(CLASSES)
MEL_IDX, NV_IDX = CLASS_TO_IDX["mel"], CLASS_TO_IDX["nv"]

print(json.dumps({k: (list(v) if isinstance(v, tuple) else str(v) if isinstance(v, Path) else v)
                  for k, v in asdict(CFG).items()}, indent=2, default=str))
print(f"\nTotal epochs per run : {CFG.total_epochs} "
      f"({CFG.stage1_epochs} frozen + {CFG.stage2_epochs} fine-tune)")
print(f"Runs planned         : n_models x {len(CFG.seeds)} seeds")
print(f"Classes ({NUM_CLASSES})          : {CLASSES}")

Dataloader workers : 8  (os.cpu_count() = 12)
Mixed precision    : enabled | dtype=torch.bfloat16 | GradScaler=no (bf16 needs none)
{
  "experiment_name": "mva_dermoscopy_benchmark_v1",
  "seeds": [
    42,
    123,
    2024,
    7,
    2718
  ],
  "split_seed": 20240101,
  "img_size": 224,
  "train_frac": 0.7,
  "val_frac": 0.15,
  "test_frac": 0.15,
  "cache_resized": true,
  "drop_exact_duplicates": false,
  "cache_short_side": 256,
  "num_workers": 8,
  "prefetch_factor": 6,
  "stage1_epochs": 4,
  "stage2_epochs": 16,
  "early_stopping_patience": 3,
  "early_stopping_min_delta": 0.0001,
  "lr_head_stage1": 0.001,
  "lr_head_stage2": 0.0001,
  "lr_backbone_vit": 1e-05,
  "lr_backbone_conv": 5e-05,
  "weight_decay": 0.0001,
  "warmup_frac": 0.1,
  "grad_clip": 1.0,
  "drop_path_rate": 0.0,
  "label_smoothing": 0.0,
  "max_batch_size": 64,
  "min_batch_size": 8,
  "amp": true,
  "lr_search": true,
  "lr_grid": [
    3e-05,
    0.0001,
    0.0003,
    0.001
  ],
  "lr_search_epochs": 

In [ ]:
# ============================================================================
# Cell 2.6 - Publication-quality figure export                        (v3, new)
# ============================================================================
# Springer asks for vector artwork (EPS/PDF) or, for bitmap line art, 1200 dpi.
# The notebook's 300 dpi PNGs are below that bar. Rather than edit ten call
# sites, Figure.savefig is wrapped once so that every "*.png" it writes is
# accompanied by a vector "*.pdf". pyplot.savefig delegates to Figure.savefig,
# so this covers both call styles. The wrapper is idempotent.
import matplotlib
from matplotlib.figure import Figure

matplotlib.rcParams.update({
    "pdf.fonttype": 42,       # embed TrueType; Springer rejects Type-3 fonts
    "ps.fonttype": 42,
    "font.family": "sans-serif",
    "font.sans-serif": ["DejaVu Sans", "Helvetica", "Arial"],
})

_ORIG_SAVEFIG = getattr(Figure.savefig, "__wrapped_original__", Figure.savefig)

def _savefig_with_vector(self, fname, **kwargs):
    res = _ORIG_SAVEFIG(self, fname, **kwargs)
    try:
        p = Path(str(fname))
        if p.suffix.lower() == ".png":
            kw = {k: v for k, v in kwargs.items() if k != "dpi"}
            _ORIG_SAVEFIG(self, p.with_suffix(".pdf"), **kw)
    except Exception as e:            # noqa: BLE001
        print(f"    [figures] vector export skipped for {fname}: "
              f"{type(e).__name__}: {e}")
    return res

_savefig_with_vector.__wrapped_original__ = _ORIG_SAVEFIG
Figure.savefig = _savefig_with_vector
print("Figure export : every *.png is now mirrored as a vector *.pdf "
      "(Type-42 fonts embedded)")


Figure export : every *.png is now mirrored as a vector *.pdf (Type-42 fonts embedded)


---
## 3. Dataset Acquisition

**No Google Drive is used anywhere.** Everything is written to `/content`, which is wiped when the
runtime is recycled; Section 18 provides a ZIP export cell so that results survive a disconnect.

### 3.1 HAM10000 acquisition strategy

HAM10000 is fetched with a three-tier fallback:

| Tier | Source | Credentials |
|---|---|---|
| 1 | **Harvard Dataverse** (`doi:10.7910/DVN/DBW86T`), the canonical archive | none |
| 2 | **Kaggle mirror** `kmader/skin-cancer-mnist-ham10000` via `kagglehub` | your own Kaggle token |
| 3 | **Manual upload** of the official ZIPs + metadata CSV | none |

Tier 1 does not hard-code file identifiers. It queries the Dataverse metadata API, discovers the
current file IDs, and downloads only `HAM10000_images_part_1.zip`, `HAM10000_images_part_2.zip`,
and `HAM10000_metadata`. Segmentation masks and other large auxiliary files are skipped.

No credentials are stored in this notebook. If you use Tier 2, `kagglehub` will prompt you, or you
may place a token in the Colab *Secrets* panel (key icon in the left sidebar).

In [ ]:
# ============================================================================
# Cell 3.1 - HAM10000 download (Dataverse -> Kaggle -> manual upload)
# ============================================================================
import requests

HAM_IMG_DIR = CFG.ham_dir / "images"
HAM_IMG_DIR.mkdir(parents=True, exist_ok=True)
HAM_META_PATH = CFG.ham_dir / "HAM10000_metadata.csv"

DATAVERSE = "https://dataverse.harvard.edu"
HAM_DOI = "doi:10.7910/DVN/DBW86T"
WANTED = ("HAM10000_images_part_1", "HAM10000_images_part_2", "HAM10000_metadata")

def _n_images() -> int:
    return len(list(HAM_IMG_DIR.glob("*.jpg"))) + len(list(HAM_IMG_DIR.glob("*.JPG")))

def _stream_download(url: str, dest: Path, params=None, chunk=1 << 20) -> bool:
    try:
        with requests.get(url, params=params, stream=True, timeout=180) as r:
            r.raise_for_status()
            total = int(r.headers.get("content-length", 0))
            done = 0
            with open(dest, "wb") as f, tqdm(total=total or None, unit="B", unit_scale=True,
                                             desc=dest.name, leave=False) as bar:
                for blk in r.iter_content(chunk_size=chunk):
                    if blk:
                        f.write(blk)
                        done += len(blk)
                        bar.update(len(blk))
        return dest.exists() and dest.stat().st_size > 0
    except Exception as e:  # noqa: BLE001
        print(f"    download failed: {type(e).__name__}: {e}")
        if dest.exists():
            dest.unlink()
        return False

def _unzip(zpath: Path, target: Path) -> int:
    with zipfile.ZipFile(zpath) as z:
        members = [m for m in z.namelist() if m.lower().endswith((".jpg", ".jpeg", ".png"))]
        for m in tqdm(members, desc=f"unzip {zpath.name}", leave=False):
            data = z.read(m)
            (target / Path(m).name).write_bytes(data)
    return len(members)

def acquire_ham_dataverse() -> bool:
    print("[Tier 1] Harvard Dataverse")
    try:
        meta = requests.get(f"{DATAVERSE}/api/datasets/:persistentId/",
                            params={"persistentId": HAM_DOI}, timeout=120).json()
        files = meta["data"]["latestVersion"]["files"]
    except Exception as e:  # noqa: BLE001
        print(f"    metadata API unreachable: {e}")
        return False
    print(f"    dataset version lists {len(files)} files")
    tmp = CFG.ham_dir / "_tmp"; tmp.mkdir(exist_ok=True)
    got_meta = HAM_META_PATH.exists()
    for f in files:
        df_ = f["dataFile"]
        label = df_.get("originalFileName") or df_["filename"]
        if not label.startswith(WANTED):
            continue
        fid = df_["id"]
        url = f"{DATAVERSE}/api/access/datafile/{fid}"
        if "metadata" in label.lower():
            if got_meta:
                continue
            print(f"    fetching {label}")
            if _stream_download(url, HAM_META_PATH, params={"format": "original"}) or \
               _stream_download(url, HAM_META_PATH):
                got_meta = True
        else:
            zpath = tmp / (label if label.endswith(".zip") else label + ".zip")
            print(f"    fetching {zpath.name}")
            if _stream_download(url, zpath, params={"format": "original"}) or \
               _stream_download(url, zpath):
                try:
                    n = _unzip(zpath, HAM_IMG_DIR)
                    print(f"      extracted {n} images")
                except zipfile.BadZipFile:
                    print("      not a valid zip - skipping")
                zpath.unlink(missing_ok=True)
    shutil.rmtree(tmp, ignore_errors=True)
    return got_meta and _n_images() > 9000

def acquire_ham_kaggle() -> bool:
    print("[Tier 2] Kaggle mirror (kmader/skin-cancer-mnist-ham10000)")
    try:
        import kagglehub
        path = Path(kagglehub.dataset_download("kmader/skin-cancer-mnist-ham10000"))
    except Exception as e:  # noqa: BLE001
        print(f"    kagglehub failed: {type(e).__name__}: {e}")
        return False
    n = 0
    for p in path.rglob("*"):
        if p.suffix.lower() in (".jpg", ".jpeg") and p.name.startswith("ISIC"):
            tgt = HAM_IMG_DIR / p.name
            if not tgt.exists():
                shutil.copy2(p, tgt); n += 1
        elif p.name.lower() in ("ham10000_metadata.csv", "ham10000_metadata"):
            shutil.copy2(p, HAM_META_PATH)
    print(f"    copied {n} images")
    return HAM_META_PATH.exists() and _n_images() > 9000

def acquire_ham_upload() -> bool:
    print("[Tier 3] Manual upload")
    print("    Upload HAM10000_images_part_1.zip, HAM10000_images_part_2.zip and")
    print("    HAM10000_metadata.csv (multi-select is allowed).")
    try:
        from google.colab import files as colab_files
    except ImportError:
        print("    not running in Colab - place the files in", CFG.ham_dir, "manually.")
        return False
    up = colab_files.upload()
    for name, blob in up.items():
        p = CFG.ham_dir / name
        p.write_bytes(blob)
        if p.suffix.lower() == ".zip":
            print(f"    extracting {name}: {_unzip(p, HAM_IMG_DIR)} images")
            p.unlink()
        elif "metadata" in name.lower():
            shutil.move(str(p), HAM_META_PATH)
    return HAM_META_PATH.exists() and _n_images() > 9000

with Timer("dataset_acquisition_ham", TIMINGS):
    if HAM_META_PATH.exists() and _n_images() > 9000:
        print("HAM10000 already present - skipping download.")
    else:
        ok = acquire_ham_dataverse() or acquire_ham_kaggle() or acquire_ham_upload()
        if not ok:
            raise RuntimeError(
                "HAM10000 could not be acquired by any tier. Obtain the files from "
                "https://doi.org/10.7910/DVN/DBW86T and re-run this cell using Tier 3.")

print(f"\nHAM10000 images  : {_n_images()}")
print(f"HAM10000 metadata: {HAM_META_PATH}  ({HAM_META_PATH.stat().st_size / 1024:.0f} KiB)")

[Tier 1] Harvard Dataverse
    metadata API unreachable: Expecting value: line 1 column 1 (char 0)
[Tier 2] Kaggle mirror (kmader/skin-cancer-mnist-ham10000)
Using Colab cache for faster access to the 'skin-cancer-mnist-ham10000' dataset.
    copied 10015 images
[timer] dataset_acquisition_ham: 84.28 s

HAM10000 images  : 10015
HAM10000 metadata: /content/data/HAM10000/HAM10000_metadata.csv  (550 KiB)


### 3.2 Building the HAM10000 index

The Dataverse copy of the metadata may be delivered as an ingested tab-separated `.tab` file
rather than the original CSV, so the delimiter is sniffed rather than assumed. We keep the columns
that matter for this study — `lesion_id` (the grouping key), `image_id`, `dx` (the label),
`dx_type`, `age`, `sex`, `localization` — and verify that every referenced image exists on disk.

In [ ]:
# ============================================================================
# Cell 3.2 - HAM10000 index + optional resize cache
# ============================================================================
def read_ham_metadata(path: Path) -> pd.DataFrame:
    for sep in (",", "\t", ";"):
        try:
            df = pd.read_csv(path, sep=sep)
            if {"image_id", "dx"}.issubset(df.columns):
                return df
        except Exception:  # noqa: BLE001
            continue
    raise ValueError(f"Could not parse HAM10000 metadata at {path}")

ham = read_ham_metadata(HAM_META_PATH)
print(f"Metadata rows: {len(ham)}   columns: {list(ham.columns)}")

# resolve file paths
by_stem = {p.stem: p for p in HAM_IMG_DIR.iterdir() if p.suffix.lower() in (".jpg", ".jpeg", ".png")}
ham["path"] = ham["image_id"].map(lambda s: str(by_stem.get(s, "")))
missing = int((ham["path"] == "").sum())
if missing:
    print(f"WARNING: {missing} metadata rows have no image file on disk and are dropped.")
    ham = ham[ham["path"] != ""].reset_index(drop=True)

# --- grouping key: lesion_id -------------------------------------------------
HAS_LESION_ID = "lesion_id" in ham.columns and ham["lesion_id"].notna().all()
if HAS_LESION_ID:
    ham["group_id"] = ham["lesion_id"].astype(str)
    GROUP_KEY, GROUP_NOTE = "lesion_id", "official lesion_id from HAM10000_metadata"
else:
    ham["group_id"] = ham["image_id"].astype(str)
    GROUP_KEY, GROUP_NOTE = "image_id", "FALLBACK: no usable lesion_id column (see Limitations)"
print(f"Grouping key : {GROUP_KEY}  ({GROUP_NOTE})")

ham["label"] = ham["dx"].astype(str).str.lower().str.strip()
unknown = sorted(set(ham["label"]) - set(CLASSES))
if unknown:
    raise ValueError(f"Unexpected diagnosis labels in metadata: {unknown}. "
                     "Labels are NEVER remapped silently - inspect the metadata file.")
ham["label_idx"] = ham["label"].map(CLASS_TO_IDX).astype(int)

# --- optional resize cache (decode-time optimisation, not augmentation) ------
if CFG.cache_resized:
    cache_dir = CFG.ham_dir / f"images_{CFG.cache_short_side}"
    cache_dir.mkdir(exist_ok=True)
    todo = [(r.path, cache_dir / (Path(r.path).stem + ".jpg")) for r in ham.itertuples()
            if not (cache_dir / (Path(r.path).stem + ".jpg")).exists()]
    if todo:
        def _resize_one(job):
            s_path, d_path = job
            with Image.open(s_path) as im:
                im = im.convert("RGB")
                w, h = im.size
                s = CFG.cache_short_side / min(w, h)
                if s < 1.0:
                    im = im.resize((max(1, round(w * s)), max(1, round(h * s))), Image.BICUBIC)
                im.save(d_path, quality=95, subsampling=0)
        # PIL releases the GIL during JPEG decode/encode, so threads scale here.
        # Serial, this loop is ~5 min of GPU-idle wall-clock on 10k images.
        with Timer("dataset_resize_cache", TIMINGS):
            with ThreadPoolExecutor(max_workers=CFG.num_workers) as ex:
                list(tqdm(ex.map(_resize_one, todo), total=len(todo),
                          desc=f"building {CFG.cache_short_side}px cache ({CFG.num_workers} threads)",
                          leave=False))
    ham["path_full"] = ham["path"]
    ham["path"] = ham["path"].map(lambda p: str(cache_dir / (Path(p).stem + ".jpg")))
    print(f"Resize cache : {cache_dir} (short side {CFG.cache_short_side}px, quality 95)")
else:
    ham["path_full"] = ham["path"]

ham = ham[["image_id", "group_id", "label", "label_idx", "path", "path_full",
           *[c for c in ("dx_type", "age", "sex", "localization") if c in ham.columns]]]
ham.to_csv(CFG.out_dir / "ham10000_index.csv", index=False)
print(f"\nIndex built: {len(ham)} images / {ham.group_id.nunique()} unique {GROUP_KEY} groups")
print(ham.head().to_string())

Metadata rows: 10015   columns: ['lesion_id', 'image_id', 'dx', 'dx_type', 'age', 'sex', 'localization']
Grouping key : lesion_id  (official lesion_id from HAM10000_metadata)


building 256px cache (8 threads):   0%|          | 0/10015 [00:00<?, ?it/s]

[timer] dataset_resize_cache: 18.14 s
Resize cache : /content/data/HAM10000/images_256 (short side 256px, quality 95)

Index built: 10015 images / 7470 unique lesion_id groups
       image_id     group_id label  label_idx                                                path                                       path_full dx_type   age   sex localization
0  ISIC_0027419  HAM_0000118   bkl          2  /content/data/HAM10000/images_256/ISIC_0027419.jpg  /content/data/HAM10000/images/ISIC_0027419.jpg   histo  80.0  male        scalp
1  ISIC_0025030  HAM_0000118   bkl          2  /content/data/HAM10000/images_256/ISIC_0025030.jpg  /content/data/HAM10000/images/ISIC_0025030.jpg   histo  80.0  male        scalp
2  ISIC_0026769  HAM_0002730   bkl          2  /content/data/HAM10000/images_256/ISIC_0026769.jpg  /content/data/HAM10000/images/ISIC_0026769.jpg   histo  80.0  male        scalp
3  ISIC_0025661  HAM_0002730   bkl          2  /content/data/HAM10000/images_256/ISIC_0025661.jpg  /content/

### 3.3 External validation set (automatic download)

External validation is the only evidence in this study that the models generalise beyond the
institution HAM10000 came from, so it should not depend on a manual upload. This section
downloads a **held-out dataset from a different hospital** straight from the ISIC Archive's
public API — no account, no licence form, no upload.

**One trap to know about.** The obvious choice, *ISIC 2019*, is an aggregate that **contains
HAM10000** (HAM10000 + BCN20000 + MSK, 25,331 images). Using it as external validation would
test the models on their own training data. The notebook therefore pulls a **single named
source collection**, and Section 5 verifies by pixel hash that not one image of it appears in
HAM10000. If any does, the audit fails and the run stops.

**Default: BCN20000** — 18,946 dermoscopic images collected 2010–2016 at Hospital Clínic,
Barcelona, released under CC BY 4.0. It is deliberately harder than a curated benchmark: it
includes lesions in awkward sites such as nails and mucosa, lesions too large for the
dermatoscope aperture, and hypopigmented lesions. That is what makes it a real domain-shift
test rather than a second easy test set.

`EXT_DATASET` selects the source. `EXT_MAX_IMAGES` caps the download with a **stratified,
seeded** subsample so the run stays affordable and reproducible; set it to `None` for the full
collection. PH2 remains available through `EXT_SOURCE_URL` or the upload prompt for anyone who
already has it.

In [ ]:
# ============================================================================
# Cell 3.3 - External validation set: automatic acquisition
# ============================================================================
EXT_DATASET = "BCN20000"     # "BCN20000" | "HIBA" | "PH2" | "NONE"
EXT_MAX_IMAGES = 4000        # None = the whole collection (BCN20000 is ~19k images / ~6 GB)
EXT_SOURCE_URL = ""          # optional: a direct archive URL you are licensed to use
EXT_TRY_UPLOAD = False       # last-resort manual upload (needed only for PH2)

# Collections are looked up by name through the API rather than hard-coded, because
# numeric collection ids change and a stale id fails as an empty result rather than
# as an error - which would silently produce "no external validation".
EXT_REGISTRY = {
    "BCN20000": {"match": ("bcn20000", "bcn 20000"),
                 "institution": "Hospital Clinic de Barcelona",
                 "licence": "CC BY 4.0", "expected": 18946},
    "HIBA":     {"match": ("hiba",),
                 "institution": "Hospital Italiano de Buenos Aires",
                 "licence": "CC BY 4.0", "expected": None},
}
EXT_NAME = EXT_DATASET
ISIC_API = "https://api.isic-archive.com/api/v2"

import urllib.request as _urq

def _api_get(url: str, timeout: int = 60):
    req = _urq.Request(url, headers={"Accept": "application/json",
                                     "User-Agent": "mva-benchmark"})
    with _urq.urlopen(req, timeout=timeout) as r:
        return json.load(r)

def isic_find_collection(match_terms) -> tuple:
    """Return (id, name) of the first public collection whose name matches."""
    url = f"{ISIC_API}/collections/?limit=100"
    seen = []
    while url:
        page = _api_get(url)
        for col in page.get("results", []):
            nm = (col.get("name") or "").lower()
            seen.append(col.get("name"))
            if any(t in nm for t in match_terms):
                return col.get("id"), col.get("name")
        url = page.get("next")
    print(f"    no collection matched {match_terms}. Public collections seen: "
          f"{len([s for s in seen if s])}")
    return None, None

def isic_list_images(collection_id: int, cap=None) -> list:
    """Page through a collection and return [{isic_id, url, metadata}, ...]."""
    url = f"{ISIC_API}/images/search/?collections={collection_id}&limit=100"
    out = []
    with tqdm(total=cap, desc="listing images", leave=False) as bar:
        while url:
            page = _api_get(url)
            for im in page.get("results", []):
                files = im.get("files") or {}
                full = (files.get("full") or {})
                if not full.get("url"):
                    continue
                out.append({"isic_id": im.get("isic_id"), "url": full["url"],
                            "metadata": im.get("metadata") or {}})
                bar.update(1)
                if cap and len(out) >= cap * 3:      # oversample, then stratify below
                    return out
            url = page.get("next")
    return out

def isic_download(records: list, target: Path) -> int:
    target.mkdir(parents=True, exist_ok=True)
    def _one(rec):
        dst = target / f"{rec['isic_id']}.jpg"
        if dst.exists() and dst.stat().st_size > 1024:
            return True
        try:
            _urq.urlretrieve(rec["url"], dst)
            return True
        except Exception:  # noqa: BLE001
            return False
    with ThreadPoolExecutor(max_workers=min(16, CFG.num_workers * 2)) as ex:
        ok = list(tqdm(ex.map(_one, records), total=len(records),
                       desc=f"downloading {EXT_NAME}", leave=False))
    return int(sum(ok))

def _ext_images_present() -> list[Path]:
    return sorted([p for p in CFG.ext_dir.rglob("*")
                   if p.suffix.lower() in (".bmp", ".png", ".jpg", ".jpeg")
                   and "lesion" not in p.parent.name.lower()
                   and "roi" not in p.parent.name.lower()
                   and "mask" not in p.stem.lower()])

EXT_META: dict[str, dict] = {}
EXT_PROVENANCE: dict = {"dataset": EXT_NAME, "route": "none"}

with Timer("dataset_acquisition_external", TIMINGS, verbose=False):
    if EXT_DATASET == "NONE":
        print("EXT_DATASET = 'NONE' - external validation deliberately skipped.")
    elif _ext_images_present():
        print(f"{EXT_NAME} already present on disk.")
        EXT_PROVENANCE["route"] = "cached"
        meta_p = CFG.ext_dir / "isic_metadata.json"
        if meta_p.exists():
            EXT_META = json.loads(meta_p.read_text())
    elif EXT_SOURCE_URL:
        print(f"Downloading {EXT_NAME} from the supplied URL ...")
        _u = EXT_SOURCE_URL
        arc = CFG.ext_dir / ("ext" + (Path(_u.split("?")[0]).suffix or ".zip"))
        arc.parent.mkdir(parents=True, exist_ok=True)
        if _stream_download(_u, arc):
            try:
                shutil.unpack_archive(str(arc), str(CFG.ext_dir))
                EXT_PROVENANCE["route"] = "user URL"
            except Exception as e:  # noqa: BLE001
                print(f"    extraction failed: {type(e).__name__}: {e}")
            arc.unlink(missing_ok=True)
    elif EXT_DATASET in EXT_REGISTRY:
        spec = EXT_REGISTRY[EXT_DATASET]
        print(f"Querying the ISIC Archive for the {EXT_NAME} collection ...")
        try:
            cid, cname = isic_find_collection(spec["match"])
            if cid is None:
                raise RuntimeError("collection not found")
            print(f"    collection {cid}: {cname}")
            recs = isic_list_images(cid, EXT_MAX_IMAGES)
            print(f"    {len(recs)} images listed")
            if EXT_MAX_IMAGES and len(recs) > EXT_MAX_IMAGES:
                # Deterministic stratified subsample on the coarse diagnosis field, so the
                # class mix of the full collection is preserved and the choice is reproducible.
                _rng = np.random.default_rng(CFG.split_seed)
                _key = [str((r["metadata"].get("clinical") or {}).get("diagnosis")
                            or (r["metadata"].get("clinical") or {}).get("diagnosis_3")
                            or "unknown") for r in recs]
                _by: dict[str, list] = {}
                for r, k in zip(recs, _key):
                    _by.setdefault(k, []).append(r)
                _keep, _frac = [], EXT_MAX_IMAGES / len(recs)
                for k, group in sorted(_by.items()):
                    n = max(1, int(round(len(group) * _frac)))
                    idx = _rng.permutation(len(group))[:n]
                    _keep += [group[j] for j in idx]
                recs = _keep[:EXT_MAX_IMAGES]
                print(f"    stratified subsample -> {len(recs)} images "
                      f"(seed {CFG.split_seed}, {len(_by)} diagnosis strata)")
            n_ok = isic_download(recs, CFG.ext_dir)
            print(f"    {n_ok}/{len(recs)} images downloaded")
            EXT_META = {r["isic_id"]: r["metadata"] for r in recs}
            (CFG.ext_dir / "isic_metadata.json").write_text(json.dumps(EXT_META))
            EXT_PROVENANCE.update(route="ISIC Archive API", collection_id=cid,
                                  collection_name=cname, institution=spec["institution"],
                                  licence=spec["licence"], n_listed=len(recs),
                                  n_downloaded=n_ok, subsampled=bool(EXT_MAX_IMAGES))
        except Exception as e:  # noqa: BLE001
            print(f"    ISIC Archive route failed: {type(e).__name__}: {e}")
            print("    Falling back: set EXT_SOURCE_URL, or EXT_TRY_UPLOAD = True, or")
            print("    EXT_DATASET = 'NONE' to proceed without external validation.")
    elif EXT_TRY_UPLOAD:
        try:
            from google.colab import files as colab_files
            print("Upload an archive of the external dataset - or Cancel to skip.")
            up = colab_files.upload()
            for name, blob in up.items():
                arc = CFG.ext_dir / name
                arc.parent.mkdir(parents=True, exist_ok=True)
                arc.write_bytes(blob)
                try:
                    shutil.unpack_archive(str(arc), str(CFG.ext_dir))
                    EXT_PROVENANCE["route"] = "manual upload"
                except Exception as e:  # noqa: BLE001
                    print(f"    extraction failed: {type(e).__name__}: {e}")
                arc.unlink(missing_ok=True)
        except Exception as e:  # noqa: BLE001
            print(f"Upload skipped ({type(e).__name__}).")

EXT_IMAGE_FILES = _ext_images_present()
EXT_AVAILABLE = len(EXT_IMAGE_FILES) > 0
print(f"\n{EXT_NAME} image files on disk: {len(EXT_IMAGE_FILES)}")
if EXT_AVAILABLE:
    print(f"  route: {EXT_PROVENANCE.get('route')}"
          + (f" | {EXT_PROVENANCE.get('institution')}" if EXT_PROVENANCE.get("institution") else "")
          + (f" | {EXT_PROVENANCE.get('licence')}" if EXT_PROVENANCE.get("licence") else ""))
else:
    print("EXTERNAL VALIDATION UNAVAILABLE -> Section 11 will print SKIPPED and Table 4 will")
    print("show N/A throughout. No cross-dataset number is ever estimated or fabricated.")


Querying the ISIC Archive for the BCN20000 collection ...
    collection 249: BCN20000


listing images:   0%|          | 0/4000 [00:00<?, ?it/s]

    12000 images listed
    stratified subsample -> 4000 images (seed 20240101, 11 diagnosis strata)


downloading BCN20000:   0%|          | 0/4000 [00:00<?, ?it/s]

    4000/4000 images downloaded

BCN20000 image files on disk: 4000
  route: ISIC Archive API | Hospital Clinic de Barcelona | CC BY 4.0


### 3.4 External index and label parsing

Two label sources are supported, and both end in the same schema (`image_id`, `path`,
`ext_label`): ISIC Archive metadata, and the PH2 annotation files. ISIC diagnosis fields have
changed shape over the years, so several key layouts are tried and whatever is found is mapped
onto HAM10000's seven-class vocabulary. Anything that does not map to a class this study
evaluates is dropped, and the count dropped is printed rather than hidden.

In [ ]:
# ============================================================================
# Cell 3.4 - External index and label parsing
# ============================================================================
PH2_CODE_TO_NAME = {0: "common_nevus", 1: "atypical_nevus", 2: "melanoma"}

# ISIC diagnosis strings -> HAM10000's seven classes. Only lesion types this study
# actually evaluates are kept; everything else is dropped and counted.
ISIC_TO_HAM = {
    "melanoma": "mel",
    "nevus": "nv", "melanocytic nevus": "nv",
    "basal cell carcinoma": "bcc",
    "actinic keratosis": "akiec", "squamous cell carcinoma": "akiec",
    "bowen's disease": "akiec", "intraepithelial carcinoma": "akiec",
    "seborrheic keratosis": "bkl", "solar lentigo": "bkl", "lentigo nos": "bkl",
    "lichenoid keratosis": "bkl", "benign keratosis": "bkl",
    "dermatofibroma": "df",
    "vascular lesion": "vasc", "angioma": "vasc", "hemangioma": "vasc",
    "angiokeratoma": "vasc", "pyogenic granuloma": "vasc",
}

def _isic_diagnosis(meta: dict) -> str:
    """Pull a diagnosis string out of any of the ISIC metadata layouts."""
    clin = meta.get("clinical") or meta
    for k in ("diagnosis", "diagnosis_3", "diagnosis_2", "diagnosis_1",
              "ben_mal", "benign_malignant"):
        v = clin.get(k)
        if isinstance(v, str) and v.strip():
            return v.strip().lower()
    return ""

def parse_ph2_txt(path: Path) -> dict:
    out = {}
    for line in path.read_text(errors="ignore").splitlines():
        if "||" not in line:
            continue
        parts = [p.strip() for p in line.split("||")]
        nm = parts[0] if parts else ""
        for p in parts[1:]:
            if p.isdigit() and nm.upper().startswith("IMD"):
                out[nm] = int(p)
                break
    return out

def parse_ph2_xlsx(path: Path) -> dict:
    try:
        df = pd.read_excel(path, header=None)
    except Exception:  # noqa: BLE001
        return {}
    out = {}
    for _, row in df.iterrows():
        vals = [v for v in row.tolist() if pd.notna(v)]
        if not vals or not str(vals[0]).upper().startswith("IMD"):
            continue
        for v in vals[1:]:
            try:
                code = int(v)
            except (TypeError, ValueError):
                continue
            if code in PH2_CODE_TO_NAME:
                out[str(vals[0]).strip()] = code
                break
    return out

recs, n_unmapped = [], 0
if EXT_AVAILABLE and EXT_META:
    # ---- ISIC Archive route --------------------------------------------------
    for p in EXT_IMAGE_FILES:
        meta = EXT_META.get(p.stem)
        if meta is None:
            continue
        dx = _isic_diagnosis(meta)
        ham_cls = next((v for k, v in ISIC_TO_HAM.items() if k in dx), None)
        if ham_cls is None:
            n_unmapped += 1
            continue
        recs.append({"image_id": p.stem, "path": str(p), "ext_label": ham_cls,
                     "ext_raw_diagnosis": dx})
elif EXT_AVAILABLE:
    # ---- PH2 route -----------------------------------------------------------
    labels = {}
    for p in CFG.ext_dir.rglob("*"):
        if p.name.lower() in ("ph2_dataset.txt",):
            labels = labels or parse_ph2_txt(p)
        elif p.name.lower() in ("ph2_dataset.xlsx",):
            labels = labels or parse_ph2_xlsx(p)
    if labels:
        for p in EXT_IMAGE_FILES:
            code = labels.get(p.stem)
            if code in PH2_CODE_TO_NAME:
                nm = PH2_CODE_TO_NAME[code]
                recs.append({"image_id": p.stem, "path": str(p),
                             "ext_label": "mel" if nm == "melanoma" else "nv",
                             "ext_raw_diagnosis": nm})
    else:
        print("Images found but no parsable annotation file "
              "(expected ISIC metadata, PH2_dataset.txt or PH2_dataset.xlsx).")

if recs:
    ext_df = pd.DataFrame(recs)
    EXT_AVAILABLE = True
    print(f"{EXT_NAME} index built: {len(ext_df)} labelled images"
          + (f"; {n_unmapped} dropped (diagnosis outside the 7 evaluated classes)"
             if n_unmapped else ""))
    print(ext_df["ext_label"].value_counts().to_string())
    ext_df.to_csv(CFG.out_dir / "external_index.csv", index=False)
else:
    ext_df = pd.DataFrame(columns=["image_id", "path", "ext_label", "ext_raw_diagnosis"])
    EXT_AVAILABLE = False
    print(f"No {EXT_NAME} image could be matched to a label -> external validation UNAVAILABLE.")

print(f"\nEXT_AVAILABLE = {EXT_AVAILABLE}")

BCN20000 index built: 3658 labelled images; 342 dropped (diagnosis outside the 7 evaluated classes)
ext_label
nv       1180
mel       999
bcc       772
akiec     346
bkl       328
df         33

EXT_AVAILABLE = True


### 3.5 Cross-dataset label mapping — **frozen before any external evaluation**

> **Note (v3).** The mapping table below is written for PH2, the fallback external
> source. The runs reported in the manuscript used **BCN20000** (`EXT_DATASET = "BCN20000"`),
> whose `mel` and `nv` labels map to the binary targets directly and whose four other
> classes are dropped. Both routes are implemented in Cell 3.5 and produce the same
> hashed mapping for `{mel, nv}`. Rewrite this subsection around whichever source you
> actually run before submitting.

HAM10000 has seven diagnostic classes; PH2 has three clinical categories. A seven-way comparison
is impossible, so Experiment B is defined as a **binary melanoma-vs-nevus task**, and the mapping
is fixed *here*, before any PH2 image is passed through any model. The mapping is hashed, and
Section 11 asserts that the hash is unchanged.

| Source | Original label | Binary target | Rationale |
|---|---|---|---|
| HAM10000 | `mel` | **1 — melanoma** | direct correspondence |
| HAM10000 | `nv` | **0 — nevus** | direct correspondence |
| HAM10000 | `akiec`, `bcc`, `bkl`, `df`, `vasc` | *excluded* | no PH2 counterpart; including them would require an unjustified merge |
| PH2 | `melanoma` (code 2) | **1 — melanoma** | direct correspondence |
| PH2 | `common_nevus` (0), `atypical_nevus` (1) | **0 — nevus** | both are melanocytic nevi; atypical nevus is a dysplastic *nevus*, not a melanoma |

**Deriving a binary decision from a 7-class head without retraining.** Two projections are
pre-registered:

* **Primary — restricted (conditional) softmax:** `s = p(mel) / (p(mel) + p(nv))`. This is the
  posterior of melanoma *conditional on the lesion being melanocytic*, which is exactly the
  assumption PH2 satisfies (PH2 contains only melanocytic lesions).
* **Secondary — marginal:** `s = p(mel)` over all seven classes, reported as a sensitivity
  analysis to show the conclusions do not depend on the projection.

For a like-for-like comparison, the *same* projection is applied to the HAM10000 test subset
restricted to `{mel, nv}`, so the reported degradation isolates domain shift rather than task
difficulty.

**Limitations of this mapping** (repeated in Section 17): PH2's atypical nevi are
histologically borderline and are the hardest negatives; PH2 has only 40 melanomas, so its
confidence intervals are wide; PH2 images were acquired with a single Tuebinger Mole Analyzer at
20x with different illumination from the ISIC-sourced HAM10000 images; and a decision threshold of
0.5 is used unchanged rather than being tuned on PH2 (tuning on PH2 would make it a validation
set, not an external test set).

In [ ]:
# ============================================================================
# Cell 3.5 - Freeze the cross-dataset label mapping
# ============================================================================
BINARY_CLASSES = ["nevus", "melanoma"]          # index 0, 1

# The external set is labelled in the same 7-class vocabulary as HAM10000, so a
# full 7-class external evaluation is possible in addition to the binary task.
# It is reported only over the classes the external set actually contains.
EXT_SEVEN_CLASS = True

LABEL_MAPPING = OrderedDict([
    ("task", "binary melanoma (1) vs nevus (0)"),
    ("ham10000_to_binary", {"mel": 1, "nv": 0}),
    ("ham10000_excluded", ["akiec", "bcc", "bkl", "df", "vasc"]),
    # Both acquisition routes in 3.4 normalise onto HAM10000's vocabulary, so one
    # mapping serves either source. For PH2 this folds common_nevus and atypical_nevus
    # together into "nv" - atypical nevi are the hard benign cases, which is worth
    # stating when reporting specificity rather than leaving implicit.
    ("ext_to_binary", {"mel": 1, "nv": 0}),
    ("ext_excluded_from_binary", ["akiec", "bcc", "bkl", "df", "vasc"]),
    ("primary_projection", "restricted softmax: p(mel) / (p(mel) + p(nv))"),
    ("secondary_projection", "marginal: p(mel) over all 7 classes"),
    ("decision_threshold", 0.5),
    ("threshold_tuned_on_external", False),
])
MAPPING_HASH = hashlib.sha256(
    json.dumps(LABEL_MAPPING, sort_keys=True).encode()).hexdigest()[:16]
(CFG.out_dir / "label_mapping.json").write_text(
    json.dumps({"mapping": LABEL_MAPPING, "sha256_16": MAPPING_HASH}, indent=2))

print("=" * 78)
print(f"CROSS-DATASET LABEL MAPPING (frozen before any {EXT_NAME} evaluation)")
print("=" * 78)
for k, v in LABEL_MAPPING.items():
    print(f"  {k:24s}: {v}")
print(f"\n  mapping SHA-256[:16]    : {MAPPING_HASH}")
print("=" * 78)

def binary_scores(probs7: np.ndarray, projection: str = "restricted") -> np.ndarray:
    """Project 7-class probabilities onto P(melanoma) without retraining."""
    if projection == "restricted":
        pm, pn = probs7[:, MEL_IDX], probs7[:, NV_IDX]
        return pm / np.clip(pm + pn, 1e-12, None)
    if projection == "marginal":
        return probs7[:, MEL_IDX]
    raise ValueError(f"unknown projection: {projection}")

CROSS-DATASET LABEL MAPPING (frozen before any BCN20000 evaluation)
  task                    : binary melanoma (1) vs nevus (0)
  ham10000_to_binary      : {'mel': 1, 'nv': 0}
  ham10000_excluded       : ['akiec', 'bcc', 'bkl', 'df', 'vasc']
  ext_to_binary           : {'mel': 1, 'nv': 0}
  ext_excluded_from_binary: ['akiec', 'bcc', 'bkl', 'df', 'vasc']
  primary_projection      : restricted softmax: p(mel) / (p(mel) + p(nv))
  secondary_projection    : marginal: p(mel) over all 7 classes
  decision_threshold      : 0.5
  threshold_tuned_on_external: False

  mapping SHA-256[:16]    : 8d75239e2426c3c1


---
## 4. Dataset Inspection

HAM10000 is severely imbalanced: melanocytic nevi (`nv`) account for roughly two thirds of the
corpus, while dermatofibroma (`df`) and vascular lesions (`vasc`) contribute barely one percent
each. Two consequences drive later design decisions:

* **Accuracy is uninformative.** A constant `nv` predictor already achieves ~67 %. Every headline
  claim in this study therefore uses **balanced accuracy** and **macro-F1**.
* **The split must be stratified**, otherwise a rare class can be absent from validation or test.

HAM10000 also contains multiple images of the *same lesion* (different magnifications, polarised
and non-polarised captures). This is the single largest leakage risk in the dataset and is handled
in Section 6.

In [ ]:
# ============================================================================
# Cell 4.1 - Table 1a: dataset statistics
# ============================================================================
def save_table(df: pd.DataFrame, name: str, caption: str = "", index: bool = False) -> pd.DataFrame:
    df.to_csv(CFG.tab_dir / f"{name}.csv", index=index)
    (CFG.tab_dir / f"{name}.md").write_text(
        (f"**{caption}**\n\n" if caption else "") + df.to_markdown(index=index))
    return df

imgs_per_group = ham.groupby("group_id").size()
tab1a = (ham.groupby("label")
           .agg(n_images=("image_id", "size"), n_lesions=("group_id", "nunique"))
           .reindex(CLASSES).reset_index())
tab1a["pct_images"] = 100 * tab1a["n_images"] / tab1a["n_images"].sum()
tab1a["pct_lesions"] = 100 * tab1a["n_lesions"] / tab1a["n_lesions"].sum()
tab1a["imgs_per_lesion"] = tab1a["n_images"] / tab1a["n_lesions"]
tab1a["description"] = tab1a["label"].map(CLASS_LONG)
tab1a = tab1a[["label", "description", "n_images", "pct_images",
               "n_lesions", "pct_lesions", "imgs_per_lesion"]]

print("=" * 96)
print("TABLE 1a - HAM10000 class distribution")
print("=" * 96)
print(tab1a.to_string(index=False, float_format=lambda v: f"{v:8.2f}"))
print("-" * 96)
print(f"{'TOTAL':<10}{'':<46}{tab1a.n_images.sum():>10}{100.0:>10.2f}"
      f"{tab1a.n_lesions.sum():>10}{100.0:>10.2f}")
print("=" * 96)
print(f"Imbalance ratio (max/min class) : {tab1a.n_images.max() / tab1a.n_images.min():.1f} : 1")
print(f"Majority-class baseline accuracy: {100 * tab1a.n_images.max() / tab1a.n_images.sum():.2f} %")
print(f"Chance balanced accuracy        : {100 / NUM_CLASSES:.2f} %")
print(f"Lesions with >1 image           : {(imgs_per_group > 1).sum()} "
      f"({100 * (imgs_per_group > 1).mean():.1f} % of lesions); "
      f"max images per lesion = {imgs_per_group.max()}")
save_table(tab1a, "table1a_dataset_statistics", "Table 1a - HAM10000 class distribution")

if EXT_AVAILABLE:
    tab1b = (ext_df.groupby("ext_label").size().rename("n_images").reset_index())
    tab1b["pct"] = 100 * tab1b.n_images / tab1b.n_images.sum()
    tab1b["binary_target"] = tab1b["ext_label"].map(LABEL_MAPPING["ext_to_binary"])
    print(f"\nTABLE 1b - {EXT_NAME} class distribution (external test only)")
    print(tab1b.to_string(index=False, float_format=lambda v: f"{v:6.2f}"))
    save_table(tab1b, "table1b_external_statistics",
               f"Table 1b - {EXT_NAME} class distribution")
else:
    print("\nTABLE 1b - external validation set: NOT AVAILABLE (skipped)")

TABLE 1a - HAM10000 class distribution
label                                   description  n_images  pct_images  n_lesions  pct_lesions  imgs_per_lesion
akiec Actinic keratosis / intraepithelial carcinoma       327        3.27        228         3.05             1.43
  bcc                          Basal cell carcinoma       514        5.13        327         4.38             1.57
  bkl                  Benign keratosis-like lesion      1099       10.97        727         9.73             1.51
   df                                Dermatofibroma       115        1.15         73         0.98             1.58
  mel                                      Melanoma      1113       11.11        614         8.22             1.81
   nv                             Melanocytic nevus      6705       66.95       5403        72.33             1.24
 vasc                               Vascular lesion       142        1.42         98         1.31             1.45
-----------------------------------------

In [ ]:
# ============================================================================
# Cell 4.2 - Class-distribution figure
# ============================================================================
fig, axes = plt.subplots(1, 3, figsize=(16, 4.4))
ax = axes[0]
ax.bar(tab1a.label, tab1a.n_images, color="#3b6ea5", edgecolor="black", linewidth=0.6)
for i, (n, p) in enumerate(zip(tab1a.n_images, tab1a.pct_images)):
    ax.text(i, n + 90, f"{n}\n{p:.1f}%", ha="center", fontsize=8)
ax.set_yscale("log"); ax.set_ylabel("Images (log scale)")
ax.set_title("HAM10000 images per class"); ax.grid(axis="y", alpha=0.3)

ax = axes[1]
counts = imgs_per_group.value_counts().sort_index()
ax.bar(counts.index.astype(str), counts.values, color="#8c6bb1", edgecolor="black", linewidth=0.6)
ax.set_xlabel(f"Images per {GROUP_KEY}"); ax.set_ylabel("Number of lesions"); ax.set_yscale("log")
ax.set_title("Multiple captures per lesion\n(the leakage risk addressed in Section 6)")
ax.grid(axis="y", alpha=0.3)

ax = axes[2]
if EXT_AVAILABLE:
    ax.bar(tab1b.ext_label, tab1b.n_images, color="#c1666b", edgecolor="black", linewidth=0.6)
    for i, n in enumerate(tab1b.n_images):
        ax.text(i, n + 1, str(n), ha="center", fontsize=9)
    ax.set_title(f"{EXT_NAME} diagnosis"); ax.set_ylabel("Images")
    ax.tick_params(axis="x", rotation=20)
else:
    ax.text(0.5, 0.5, "external set not available", ha="center", va="center", fontsize=13)
    ax.set_axis_off()
ax.grid(axis="y", alpha=0.3)
plt.tight_layout()
plt.savefig(CFG.fig_dir / "figure0_dataset_distribution.png", dpi=300, bbox_inches="tight")
plt.show()

---
## 5. Data Leakage Audit

Leakage is the dominant source of over-optimistic results in dermoscopy benchmarks. This section
implements a **two-phase audit**:

* **Phase 1 (this section, pre-split)** — content-level checks that do not depend on the split:
  duplicate filenames, byte-identical files, perceptually identical files (SHA-256 of decoded
  pixels), metadata integrity, and label consistency within a lesion group.
* **Phase 2 (Section 6, post-split)** — partition-level checks: lesion overlap between splits,
  image overlap, duplicate-hash straddling, augmentation leakage, and test-set access control.

A consolidated **PASS/FAIL** report is printed at the end of Section 6. Any `FAIL` raises an
exception; the notebook will not train on a leaking split.

In [ ]:
AUDIT: dict[str, dict] = OrderedDict()

def record(check: str, passed: bool, detail: str, blocking: bool = True) -> None:
    """Record an audit result.

    blocking=True  -> PASS / FAIL, and a FAIL stops the run.
    blocking=False -> PASS / INFO. INFO means the condition was observed but is
                      not by itself evidence of leakage; a separate blocking check
                      tests the consequence that would matter.
    """
    status = "PASS" if passed else ("FAIL" if blocking else "INFO")
    AUDIT[check] = {"status": status, "detail": detail}
    print(f"  [{status}] {check:<42} {detail}")

def sha256_bytes(path: str, chunk: int = 1 << 20) -> str:
    h = hashlib.sha256()
    with open(path, "rb") as f:
        for blk in iter(lambda: f.read(chunk), b""):
            h.update(blk)
    return h.hexdigest()

def sha256_pixels(path: str) -> str:
    """Hash of decoded RGB pixels: catches re-encoded / re-compressed duplicates."""
    with Image.open(path) as im:
        arr = np.asarray(im.convert("RGB").resize((128, 128), Image.BILINEAR))
    return hashlib.sha256(arr.tobytes()).hexdigest()

print("=" * 90)
print("DATA LEAKAGE AUDIT - PHASE 1 (content level, pre-split)")
print("=" * 90)

with Timer("leakage_audit_phase1", TIMINGS, verbose=False):
    # 1. unique image ids
    dup_ids = ham.image_id.duplicated().sum()
    record("unique image_id", dup_ids == 0, f"{dup_ids} duplicated ids")

    # 2. every file exists and is readable
    unreadable = [p for p in ham.path.head(200) if not Path(p).exists()]
    record("image files present", len(unreadable) == 0,
           f"{len(unreadable)} unreadable in a 200-file probe")

    # 3. byte-identical files
    _paths = ham.path.tolist()
    with ThreadPoolExecutor(max_workers=CFG.num_workers) as ex:
        file_hashes = list(tqdm(ex.map(sha256_bytes, _paths), total=len(_paths),
                                desc="file hashes", leave=False))
    ham["file_sha256"] = file_hashes
    dup_file = ham[ham.file_sha256.duplicated(keep=False)]
    # HAM10000 legitimately contains several images of one lesion (26 % of lesions),
    # and a byte-identical pair is the degenerate case of that. What would actually
    # leak is a duplicate SPANNING lesions, or a duplicate straddling partitions.
    # Both are tested separately - the first immediately below, the second in Phase 2.
    # Failing merely because a duplicate exists would block the run on a condition
    # that the lesion-disjoint split already neutralises.
    n_dup_groups = dup_file.file_sha256.nunique()
    record("byte-identical duplicate files", len(dup_file) == 0,
           f"{n_dup_groups} hash groups covering {len(dup_file)} images"
           + ("" if len(dup_file) == 0 else " (informational; see the two checks below)"),
           blocking=False)
    if len(dup_file):
        _cross = dup_file.groupby("file_sha256")["group_id"].nunique()
        _n_cross = int((_cross > 1).sum())
        record("byte-duplicates confined to one lesion", _n_cross == 0,
               f"{_n_cross}/{n_dup_groups} duplicate groups span more than one lesion_id"
               + ("" if _n_cross == 0 else " - merged into one split group below"),
               blocking=False)
        _ex = (dup_file.sort_values("file_sha256")
                       .groupby("file_sha256")["image_id"].apply(list).head(5))
        for _h, _imgs in _ex.items():
            _les = sorted(dup_file[dup_file.file_sha256 == _h].group_id.unique())
            print(f"        {_h[:12]}  {_imgs}  lesion(s): {_les}")

    if CFG.drop_exact_duplicates and len(dup_file):
        _before = len(ham)
        ham = ham.drop_duplicates(subset="file_sha256", keep="first").reset_index(drop=True)
        _paths = ham.path.tolist()
        print(f"        CFG.drop_exact_duplicates=True -> dropped {_before - len(ham)} "
              f"redundant copies; {len(ham)} images remain")

    # 4. pixel-identical (re-encoded) duplicates
    with ThreadPoolExecutor(max_workers=CFG.num_workers) as ex:
        pix_hashes = list(tqdm(ex.map(sha256_pixels, _paths), total=len(_paths),
                               desc="pixel hashes", leave=False))
    ham["pixel_sha256"] = pix_hashes
    dup_pix = ham[ham.pixel_sha256.duplicated(keep=False)].sort_values("pixel_sha256")
    n_pix_groups = dup_pix.pixel_sha256.nunique()
    record("pixel-identical duplicates", True,
           f"{n_pix_groups} groups / {len(dup_pix)} images (informational; handled by grouping)")

    # 5. label consistency within a lesion group
    inconsistent = ham.groupby("group_id")["label"].nunique()
    n_bad = int((inconsistent > 1).sum())
    record("label consistent within lesion", n_bad == 0, f"{n_bad} groups with conflicting dx")

    # 6. the external set must be disjoint from HAM10000 (pixel hash)
    if EXT_AVAILABLE:
        ext_pix = {sha256_pixels(p) for p in ext_df.path.tolist()}
        overlap = len(ext_pix & set(ham.pixel_sha256))
        record(f"{EXT_NAME} disjoint from HAM10000", overlap == 0,
           f"{overlap} shared pixel hashes"
           + ("" if overlap == 0 else " - the external set contains HAM10000 images, "
                                       "so it is NOT external"))
    else:
        record("external set disjoint from HAM10000", True,
           "N/A - no external dataset loaded")

# duplicates that also share a lesion group are expected (same lesion, same capture pipeline);
# duplicates ACROSS groups would be a genuine annotation problem.
if len(dup_pix):
    cross = dup_pix.groupby("pixel_sha256")["group_id"].nunique()
    n_cross = int((cross > 1).sum())
    print(f"\n  Note: {n_cross} pixel-hash groups span more than one {GROUP_KEY}. "
          f"These are merged into a single split group below so that they cannot straddle "
          f"partitions.")
    if n_cross:
        h2g = dup_pix[dup_pix.pixel_sha256.isin(cross[cross > 1].index)]
        # Union-find. A plain dict is WRONG here: if hash A links {g1,g2} and hash B
        # links {g2,g3}, a dict leaves g1 and g3 in different split groups even though
        # they are transitively pixel-identical, which reopens the leakage hole this
        # merge exists to close.
        parent: dict[str, str] = {}
        def _find(a):
            parent.setdefault(a, a)
            while parent[a] != a:
                parent[a] = parent[parent[a]]
                a = parent[a]
            return a
        def _union(a, b):
            ra, rb = _find(a), _find(b)
            if ra != rb:
                lo, hi = sorted((ra, rb))
                parent[hi] = lo
        for _h, grp in h2g.groupby("pixel_sha256"):
            gids = sorted(grp.group_id.unique())
            for g in gids[1:]:
                _union(gids[0], g)
        n_before = ham.group_id.nunique()
        ham["group_id"] = ham["group_id"].map(lambda g: _find(g) if g in parent else g)
        n_after = ham.group_id.nunique()
        # verify transitive closure: no pixel hash may still span >1 group
        recheck = ham[ham.pixel_sha256.duplicated(keep=False)] \
                     .groupby("pixel_sha256")["group_id"].nunique()
        still = int((recheck > 1).sum())
        record("duplicate merge is transitively closed", still == 0,
               f"{still} pixel hashes still span multiple groups after union-find")
        print(f"  -> {n_before - n_after} lesion groups absorbed; "
              f"{n_after} split groups remain.")

DATA LEAKAGE AUDIT - PHASE 1 (content level, pre-split)
  [PASS] unique image_id                            0 duplicated ids
  [PASS] image files present                        0 unreadable in a 200-file probe


file hashes:   0%|          | 0/10015 [00:00<?, ?it/s]

  [INFO] byte-identical duplicate files             2 hash groups covering 4 images (informational; see the two checks below)
  [PASS] byte-duplicates confined to one lesion     0/2 duplicate groups span more than one lesion_id
        2f380821ac0e  ['ISIC_0029861', 'ISIC_0024366']  lesion(s): ['HAM_0002300']
        dbecf045aa1d  ['ISIC_0029938', 'ISIC_0024777']  lesion(s): ['HAM_0001895']


pixel hashes:   0%|          | 0/10015 [00:00<?, ?it/s]

  [PASS] pixel-identical duplicates                 2 groups / 4 images (informational; handled by grouping)
  [PASS] label consistent within lesion             0 groups with conflicting dx
  [PASS] BCN20000 disjoint from HAM10000            0 shared pixel hashes

  Note: 0 pixel-hash groups span more than one lesion_id. These are merged into a single split group below so that they cannot straddle partitions.


---
## 6. Lesion-Disjoint Splitting

### 6.1 Why a naive image-level split is invalid here

HAM10000 contains several captures of the same physical lesion. A random image-level split places
near-duplicate views of one lesion in both train and test, which inflates test accuracy by several
points and makes cross-study comparison meaningless. We therefore split at the **group** level.

### 6.2 Grouping key and its limitation

The official HAM10000 metadata provides `lesion_id` but **no patient identifier**. A single patient
may contribute several distinct lesions, so a lesion-disjoint split is *not* guaranteed to be
patient-disjoint. This is a real limitation of the public release, it is stated explicitly in
Section 17, and `lesion_id` is the strongest grouping the official metadata supports. Any
pixel-identical images that spanned two `lesion_id`s were merged into one group in Section 5, so
the effective grouping is at least as strict as `lesion_id`.

### 6.3 Algorithm

`StratifiedGroupKFold(n_splits=20)` yields twenty group-disjoint folds that are simultaneously
stratified by diagnosis. Fourteen folds form the training set (70 %), three the validation set
(15 %), and three the test set (15 %). The split is generated once with `split_seed = 20240101`
and is **shared by every model and every seed** — this is what makes the paired McNemar test in
Section 12 valid, since all models are evaluated on the identical test examples.

In [ ]:
# ============================================================================
# Cell 6.1 - Lesion-disjoint stratified split
# ============================================================================
N_FOLDS = 20
FOLDS_TRAIN, FOLDS_VAL, FOLDS_TEST = 14, 3, 3
assert FOLDS_TRAIN + FOLDS_VAL + FOLDS_TEST == N_FOLDS

sgkf = StratifiedGroupKFold(n_splits=N_FOLDS, shuffle=True, random_state=CFG.split_seed)
fold_id = np.zeros(len(ham), dtype=int)
for k, (_, idx) in enumerate(sgkf.split(ham, ham.label_idx.values, groups=ham.group_id.values)):
    fold_id[idx] = k
ham["fold"] = fold_id

def _assign(f: int) -> str:
    if f < FOLDS_TRAIN:
        return "train"
    if f < FOLDS_TRAIN + FOLDS_VAL:
        return "val"
    return "test"

ham["split"] = ham.fold.map(_assign)
train_df = ham[ham.split == "train"].reset_index(drop=True)
val_df   = ham[ham.split == "val"].reset_index(drop=True)
test_df  = ham[ham.split == "test"].reset_index(drop=True)

SPLIT_HASH = hashlib.sha256(
    "|".join(sorted(f"{r.image_id}:{r.split}" for r in ham.itertuples())).encode()
).hexdigest()[:16]

tab1c = pd.DataFrame({
    "split": ["train", "val", "test"],
    "images": [len(train_df), len(val_df), len(test_df)],
    "lesions": [train_df.group_id.nunique(), val_df.group_id.nunique(), test_df.group_id.nunique()],
})
tab1c["pct_images"] = 100 * tab1c.images / len(ham)
for c in CLASSES:
    tab1c[c] = [int((d.label == c).sum()) for d in (train_df, val_df, test_df)]

print("=" * 100)
print(f"TABLE 1c - Lesion-disjoint split (grouping key = {GROUP_KEY}, split_seed = {CFG.split_seed})")
print("=" * 100)
print(tab1c.to_string(index=False, float_format=lambda v: f"{v:7.2f}"))
print(f"\nSplit fingerprint (SHA-256[:16]): {SPLIT_HASH}")
print("\nPer-class share within each split (%):")
share = pd.DataFrame({
    s: (d.label.value_counts(normalize=True).reindex(CLASSES).fillna(0) * 100).round(2)
    for s, d in (("train", train_df), ("val", val_df), ("test", test_df))
})
share["overall"] = (ham.label.value_counts(normalize=True).reindex(CLASSES) * 100).round(2)
print(share.to_string())
save_table(tab1c, "table1c_split_distribution", "Table 1c - Lesion-disjoint split")
ham.to_csv(CFG.out_dir / "ham10000_split.csv", index=False)

TABLE 1c - Lesion-disjoint split (grouping key = lesion_id, split_seed = 20240101)
split  images  lesions  pct_images  akiec  bcc  bkl  df  mel   nv  vasc
train    7009     5232       69.99    253  345  768  70  761 4711   101
  val    1498     1120       14.96     32   84  193  24  185  955    25
 test    1508     1118       15.06     42   85  138  21  167 1039    16

Split fingerprint (SHA-256[:16]): 15d11636eef01b57

Per-class share within each split (%):
       train    val   test  overall
label                              
akiec   3.61   2.14   2.79     3.27
bcc     4.92   5.61   5.64     5.13
bkl    10.96  12.88   9.15    10.97
df      1.00   1.60   1.39     1.15
mel    10.86  12.35  11.07    11.11
nv     67.21  63.75  68.90    66.95
vasc    1.44   1.67   1.06     1.42


In [ ]:
# ============================================================================
# Cell 6.2 - Phase 2 audit + consolidated PASS/FAIL report
# ============================================================================
print("=" * 90)
print("DATA LEAKAGE AUDIT - PHASE 2 (partition level, post-split)")
print("=" * 90)

g_tr, g_va, g_te = (set(d.group_id) for d in (train_df, val_df, test_df))
i_tr, i_va, i_te = (set(d.image_id) for d in (train_df, val_df, test_df))

record("train/test lesion overlap = 0",  len(g_tr & g_te) == 0, f"{len(g_tr & g_te)} shared lesions")
record("train/val lesion overlap = 0",   len(g_tr & g_va) == 0, f"{len(g_tr & g_va)} shared lesions")
record("val/test lesion overlap = 0",    len(g_va & g_te) == 0, f"{len(g_va & g_te)} shared lesions")
record("train/test image overlap = 0",   len(i_tr & i_te) == 0, f"{len(i_tr & i_te)} shared images")
record("train/val image overlap = 0",    len(i_tr & i_va) == 0, f"{len(i_tr & i_va)} shared images")
record("val/test image overlap = 0",     len(i_va & i_te) == 0, f"{len(i_va & i_te)} shared images")

straddle = ham.groupby("pixel_sha256")["split"].nunique()
n_straddle = int((straddle > 1).sum())
record("no duplicate image straddles splits", n_straddle == 0,
       f"{n_straddle} pixel-hash groups appear in >1 split")

record("all classes present in every split",
       all(set(d.label) == set(CLASSES) for d in (train_df, val_df, test_df)),
       "; ".join(f"{s}={len(set(d.label))}/7" for s, d in
                 (("train", train_df), ("val", val_df), ("test", test_df))))

ratios = [len(train_df) / len(ham), len(val_df) / len(ham), len(test_df) / len(ham)]
record("split ratios within +/-3 pp of target",
       all(abs(a - b) < 0.03 for a, b in zip(ratios, [CFG.train_frac, CFG.val_frac, CFG.test_frac])),
       " / ".join(f"{100 * r:.1f}%" for r in ratios))

# --- test-set access control -------------------------------------------------
class TestSetGuard:
    """Raises if the test partition is touched before training has finished."""
    def __init__(self):
        self.training_complete = False
        self.access_log: list[tuple[str, float]] = []
    def authorise(self, purpose: str) -> None:
        if not self.training_complete:
            raise RuntimeError(
                f"TEST-SET LEAK BLOCKED: '{purpose}' attempted to read the test partition before "
                "training finished. Model selection must use the validation split only.")
        self.access_log.append((purpose, time.perf_counter() - NOTEBOOK_T0))
    def report(self) -> str:
        return f"{len(self.access_log)} authorised access(es) after training: " + \
               ", ".join(p for p, _ in self.access_log[:6]) + \
               (" ..." if len(self.access_log) > 6 else "")

GUARD = TestSetGuard()
record("test-set access guard installed", True, "model selection restricted to validation macro-F1")

print("\n" + "=" * 90)
n_fail = sum(1 for v in AUDIT.values() if v["status"] == "FAIL")
n_info = sum(1 for v in AUDIT.values() if v["status"] == "INFO")
print(f"LEAKAGE AUDIT RESULT: {len(AUDIT) - n_fail - n_info} passed, "
      f"{n_info} informational, {n_fail} FAILED")
print("=" * 90)
audit_df = pd.DataFrame([{"check": k, "status": v["status"], "detail": v["detail"]}
                         for k, v in AUDIT.items()])
save_table(audit_df, "table_leakage_audit", "Data leakage audit")
if n_info:
    print("Informational findings (observed, not blocking):")
    print(audit_df[audit_df.status == "INFO"].to_string(index=False))
if n_fail:
    print(audit_df[audit_df.status == "FAIL"].to_string(index=False))
    raise RuntimeError(f"{n_fail} leakage check(s) FAILED - refusing to train on this split.")
print("\nOVERALL: PASS - the split is lesion-disjoint, stratified, and test-isolated.")

DATA LEAKAGE AUDIT - PHASE 2 (partition level, post-split)
  [PASS] train/test lesion overlap = 0              0 shared lesions
  [PASS] train/val lesion overlap = 0               0 shared lesions
  [PASS] val/test lesion overlap = 0                0 shared lesions
  [PASS] train/test image overlap = 0               0 shared images
  [PASS] train/val image overlap = 0                0 shared images
  [PASS] val/test image overlap = 0                 0 shared images
  [PASS] no duplicate image straddles splits        0 pixel-hash groups appear in >1 split
  [PASS] all classes present in every split         train=7/7; val=7/7; test=7/7
  [PASS] split ratios within +/-3 pp of target      70.0% / 15.0% / 15.1%
  [PASS] test-set access guard installed            model selection restricted to validation macro-F1

LEAKAGE AUDIT RESULT: 16 passed, 1 informational, 0 FAILED
Informational findings (observed, not blocking):
                         check status                                    

---
## 7. Model Definitions

### 7.1 Common design

To make the comparison about the **backbone** and nothing else, every architecture is wrapped in
the identical classifier:

```
backbone -> pooled feature vector f in R^D -> LayerNorm(D) -> Dropout(0.1) -> Linear(D, 7)
```

Nothing else differs: identical input resolution, identical augmentation, identical loss,
identical optimiser family, identical schedule, identical split, identical seeds. Where the
official pretraining used a non-ImageNet normalisation, the model's own preprocessing statistics
are used — this is a property of the released weights, not a tuning knob.

### 7.2 The four backbones and their provenance

| # | Model | Source of weights | Pretraining | Risk |
|---|---|---|---|---|
| 1 | **DINOv3 ViT-S/16** | `facebook/dinov3-vits16-pretrain-lvd1689m` (HF, **gated**) | self-supervised, LVD-1689M | needs an accepted licence + HF token |
| 2 | **ConvNeXt V2-Tiny** | `timm: convnextv2_tiny.fcmae_ft_in22k_in1k` | FCMAE + IN-22k/IN-1k supervised FT | low |
| 3 | **MambaVision-T** | `nvidia/MambaVision-T-1K` (HF, `trust_remote_code`) | ImageNet-1k supervised | needs `mamba_ssm` CUDA extension |
| 4 | **Vision-RWKV-T** | `OpenGVLab/Vision-RWKV` official code + checkpoint | ImageNet-1k supervised | JIT-compiles a custom CUDA kernel |

**Policy on failure.** Each builder either returns the *official* architecture with *official*
pretrained weights, or raises. There is no silent substitution. A documented, opt-in fallback
exists only for DINOv3 (see 7.3); if used, it is renamed everywhere to
`DINOv2-ViT-S/14 [FALLBACK]` so that no table can be misread.

### 7.3 DINOv3 access

The DINOv3 repository is gated on Hugging Face. Accept the licence at
`huggingface.co/facebook/dinov3-vits16-pretrain-lvd1689m`, create a read token, and store it in
the Colab **Secrets** panel under the name `HF_TOKEN` (no credential is written into this
notebook). If the token is absent or the licence is not accepted, the builder raises a descriptive
error. Setting `ALLOW_DINOV3_FALLBACK = True` then permits the closest reproducible
self-supervised alternative — DINOv2 ViT-S/14 — which is *labelled as such in every output*.

In [ ]:
# ============================================================================
# Cell 7.1 - Authentication (no credentials stored in the notebook)
# ============================================================================
ALLOW_DINOV3_FALLBACK = False   # opt-in; the fallback is renamed in every table if used

HF_TOKEN = os.environ.get("HF_TOKEN") or os.environ.get("HUGGINGFACE_TOKEN")
if not HF_TOKEN:
    try:
        from google.colab import userdata
        HF_TOKEN = userdata.get("HF_TOKEN")
    except Exception:  # noqa: BLE001
        HF_TOKEN = None

if HF_TOKEN:
    os.environ["HF_TOKEN"] = HF_TOKEN
    try:
        from huggingface_hub import login
        login(token=HF_TOKEN, add_to_git_credential=False)
        print("Hugging Face: authenticated (token read from environment/Colab Secrets).")
    except Exception as e:  # noqa: BLE001
        print(f"Hugging Face login failed: {e}")
else:
    print("Hugging Face: NO token found.")
    print("  -> DINOv3 (gated) will fail unless you add HF_TOKEN to Colab Secrets.")
    print("  -> ConvNeXt V2 and MambaVision are ungated and unaffected.")

Hugging Face: NO token found.
  -> DINOv3 (gated) will fail unless you add HF_TOKEN to Colab Secrets.
  -> ConvNeXt V2 and MambaVision are ungated and unaffected.


In [ ]:
# ============================================================================
# Cell 7.2 - Uniform classifier wrapper + freeze/unfreeze utilities
# ============================================================================
IMAGENET_MEAN, IMAGENET_STD = (0.485, 0.456, 0.406), (0.229, 0.224, 0.225)

class LesionClassifier(nn.Module):
    """backbone -> pooled features -> LayerNorm -> Dropout -> Linear(num_classes)."""
    def __init__(self, backbone: nn.Module, feat_dim: int, num_classes: int, dropout: float = 0.1):
        super().__init__()
        self.backbone = backbone
        self.feat_dim = feat_dim
        self.head = nn.Sequential(nn.LayerNorm(feat_dim), nn.Dropout(dropout),
                                  nn.Linear(feat_dim, num_classes))
        nn.init.trunc_normal_(self.head[2].weight, std=0.01)
        nn.init.zeros_(self.head[2].bias)

    def forward(self, x):
        return self.head(self.backbone(x))

    def set_backbone_trainable(self, flag: bool) -> None:
        for p in self.backbone.parameters():
            p.requires_grad = flag
        self.backbone.train(flag)

    def param_groups(self, lr_backbone: float, lr_head: float, weight_decay: float):
        """No weight decay on norms/biases - standard practice for ViT/ConvNeXt fine-tuning."""
        def split(module):
            decay, no_decay = [], []
            for n, p in module.named_parameters():
                if not p.requires_grad:
                    continue
                (no_decay if (p.ndim <= 1 or n.endswith(".bias")) else decay).append(p)
            return decay, no_decay
        bd, bn = split(self.backbone)
        hd, hn = split(self.head)
        groups = []
        if bd: groups.append({"params": bd, "lr": lr_backbone, "weight_decay": weight_decay})
        if bn: groups.append({"params": bn, "lr": lr_backbone, "weight_decay": 0.0})
        if hd: groups.append({"params": hd, "lr": lr_head, "weight_decay": weight_decay})
        if hn: groups.append({"params": hn, "lr": lr_head, "weight_decay": 0.0})
        return groups

def infer_feature_dim(backbone: nn.Module, img_size: int, device=None) -> int:
    """Probe the pooled feature width. Runs on `device` because the selective-scan (MambaVision)
    and WKV (Vision-RWKV) kernels are CUDA-only and would crash on CPU."""
    device = device or DEVICE
    backbone = backbone.to(device)
    backbone.eval()
    with torch.no_grad():
        out = backbone(torch.zeros(2, 3, img_size, img_size, device=device))
    if out.ndim != 2:
        raise ValueError(f"backbone must return [B, D]; got shape {tuple(out.shape)}")
    return int(out.shape[1])

In [ ]:
# ============================================================================
# Cell 7.3 - Backbone builders (official implementations only)
# ============================================================================
import timm
from transformers import AutoModel, AutoConfig

# ---------------------------------------------------------------- DINOv3 ----
class DinoV3Features(nn.Module):
    """CLS token concatenated with the mean of the patch tokens (registers excluded).

    timm reports `num_prefix_tokens` (CLS + registers) directly, so the split is read
    from the model rather than guessed from a config field that may be named differently.
    A wrong register count would silently average the wrong tokens and no downstream
    metric would reveal it, so the layout is still asserted on the first forward pass.
    """
    def __init__(self, model, patch_size: int = 16):
        super().__init__()
        self.model = model
        self.n_prefix = int(getattr(model, "num_prefix_tokens", 1))
        self.patch_size = patch_size
        self._checked = False
    def forward(self, x):
        h = self.model.forward_features(x)            # [B, prefix + N, C]
        if not self._checked:
            self._verify(h, x)
        cls = h[:, 0]
        patches = h[:, self.n_prefix:].mean(dim=1)
        return torch.cat([cls, patches], dim=-1)

    def _verify(self, h, x) -> None:
        n_patches = (x.shape[-2] // self.patch_size) * (x.shape[-1] // self.patch_size)
        expected = self.n_prefix + n_patches
        if h.shape[1] != expected:
            raise RuntimeError(
                f"DINOv3 token layout mismatch: got {h.shape[1]} tokens, expected "
                f"{self.n_prefix} prefix (CLS + registers) + {n_patches} patch = {expected}. "
                "The CLS/patch split would be silently wrong.")
        self._checked = True
        print(f"    [dinov3] token layout verified: {self.n_prefix} prefix "
              f"(1 CLS + {self.n_prefix - 1} register) + {n_patches} patch tokens, "
              f"width {h.shape[-1]} -> feature dim {2 * h.shape[-1]}")


class TimmFeatures(nn.Module):
    def __init__(self, model):
        super().__init__()
        self.model = model
    def forward(self, x):
        f = self.model(x)
        if f.ndim == 4:
            f = f.mean(dim=(2, 3))
        elif f.ndim == 3:
            f = f.mean(dim=1)
        return f

DINOV3_TIMM = "vit_small_patch16_dinov3.lvd1689m"   # ungated mirror of the same weights
DINOV3_GATED = "facebook/dinov3-vits16-pretrain-lvd1689m"

def build_dinov3(img_size: int):
    """DINOv3 ViT-S/16, distilled on LVD-1689M.

    Route 1 (default) is timm's republication of Meta's weights, which needs no token and
    no licence acceptance. Two documented differences from the original release, both
    recorded in the manifest rather than glossed over:
      * QKV biases are disabled instead of loaded, because the released biases are all
        zero - functionally identical;
      * RoPE periods are generated in float32 rather than kept as a bfloat16 buffer,
        which introduces small numerical differences.
    Route 2 is the original gated repository, used only if route 1 fails and a token is
    present. Route 3 is the DINOv2 fallback, and it is off by default because it is a
    different model and would change what the study can claim.
    """
    try:
        m = timm.create_model(DINOV3_TIMM, pretrained=True, num_classes=0,
                              img_size=img_size)
        return (DinoV3Features(m, patch_size=16), "DINOv3 ViT-S/16",
                f"timm:{DINOV3_TIMM}", IMAGENET_MEAN, IMAGENET_STD, False)
    except Exception as e_timm:  # noqa: BLE001
        print(f"    [dinov3] timm route failed: {type(e_timm).__name__}: "
              f"{str(e_timm)[:160]}")

    try:
        cfg = AutoConfig.from_pretrained(DINOV3_GATED, token=HF_TOKEN)
        model = AutoModel.from_pretrained(DINOV3_GATED, token=HF_TOKEN)
        n_reg = int(getattr(cfg, "num_register_tokens", 4) or 0)
        class _HFWrap(nn.Module):
            def __init__(self, mdl, n_prefix):
                super().__init__()
                self.mdl, self.num_prefix_tokens = mdl, n_prefix
            def forward_features(self, x):
                return self.mdl(pixel_values=x).last_hidden_state
        wrapped = _HFWrap(model, 1 + n_reg)
        print("    [dinov3] loaded from the gated repository via HF_TOKEN")
        return (DinoV3Features(wrapped, patch_size=16), "DINOv3 ViT-S/16",
                DINOV3_GATED, IMAGENET_MEAN, IMAGENET_STD, False)
    except Exception as e_hf:  # noqa: BLE001
        msg = (f"DINOv3 could not be loaded.\n"
               f"    timm route  : failed (see above)\n"
               f"    gated route : {type(e_hf).__name__}: {str(e_hf)[:200]}")
        if not ALLOW_DINOV3_FALLBACK:
            raise RuntimeError(
                msg + "\n    Set ALLOW_DINOV3_FALLBACK = True to substitute DINOv2 ViT-S/14 "
                      "(a DIFFERENT model, labelled [FALLBACK] in every table).")
        print(msg)
        print("    -> DOCUMENTED FALLBACK: DINOv2 ViT-S/14 (self-supervised, LVD-142M).")
        m = timm.create_model("vit_small_patch14_dinov2.lvd142m", pretrained=True,
                              num_classes=0, img_size=img_size, dynamic_img_size=True)
        return (TimmFeatures(m), "DINOv2-ViT-S/14 [FALLBACK]",
                "timm:vit_small_patch14_dinov2.lvd142m", IMAGENET_MEAN, IMAGENET_STD, True)

# ------------------------------------------------------------ ConvNeXt V2 ----
def build_convnextv2(img_size: int):
    name = "convnextv2_tiny.fcmae_ft_in22k_in1k"
    m = timm.create_model(name, pretrained=True, num_classes=0)
    dcfg = m.default_cfg
    return (TimmFeatures(m), "ConvNeXt V2-Tiny", f"timm:{name}",
            tuple(dcfg.get("mean", IMAGENET_MEAN)), tuple(dcfg.get("std", IMAGENET_STD)), False)

# ------------------------------------------------------------ MambaVision ----
class MambaVisionFeatures(nn.Module):
    """NVIDIA's HF model returns (avg_pool_features, stage_features)."""
    def __init__(self, model):
        super().__init__()
        self.model = model
    def forward(self, x):
        out = self.model(x)
        if isinstance(out, (tuple, list)):
            out = out[0]
        if hasattr(out, "last_hidden_state"):
            out = out.last_hidden_state
        if out.ndim == 4:
            out = out.mean(dim=(2, 3))
        elif out.ndim == 3:
            out = out.mean(dim=1)
        return out

def build_mambavision(img_size: int):
    repo = "nvidia/MambaVision-T-1K"
    try:
        import mamba_ssm  # noqa: F401
    except Exception as e:  # noqa: BLE001
        raise RuntimeError(
            f"MambaVision requires the `mamba_ssm` CUDA extension, which is not importable "
            f"({type(e).__name__}: {e}). Re-run Cell 2.3 with a matching prebuilt wheel or set "
            "ALLOW_MAMBA_SOURCE_BUILD = True. MambaVision will NOT be replaced by another "
            "architecture.") from e
    model = AutoModel.from_pretrained(repo, trust_remote_code=True, token=HF_TOKEN)
    return (MambaVisionFeatures(model), "MambaVision-T", repo,
            IMAGENET_MEAN, IMAGENET_STD, False)

# ------------------------------------------------------------ Vision-RWKV ----
VRWKV_REPO = "https://github.com/OpenGVLab/Vision-RWKV.git"
VRWKV_HF = "OpenGVLab/Vision-RWKV"

def _install_mm_shims():
    """Minimal stand-ins for the few mmcv/mmengine symbols the official VRWKV file imports.

    This lets us run the OFFICIAL backbone source unmodified in architecture, without pulling in
    the full mmcv/mmpretrain stack (which does not build reliably on current Colab images).
    """
    import types
    from timm.layers import DropPath, trunc_normal_

    class BaseModule(nn.Module):
        def __init__(self, init_cfg=None, *a, **k):
            super().__init__()
            self.init_cfg = init_cfg
        def init_weights(self):
            pass

    class PatchEmbed(nn.Module):
        """mmcv.cnn.bricks.transformer.PatchEmbed - conv projection returning (x, (H, W))."""
        def __init__(self, in_channels=3, embed_dims=768, conv_type="Conv2d", kernel_size=16,
                     stride=16, padding=0, dilation=1, bias=True, norm_cfg=None,
                     input_size=None, init_cfg=None, **kw):
            super().__init__()
            self.embed_dims = embed_dims
            self.projection = nn.Conv2d(in_channels, embed_dims, kernel_size=kernel_size,
                                        stride=stride, padding=padding, dilation=dilation, bias=bias)
            self.norm = nn.LayerNorm(embed_dims) if norm_cfg else None
        def forward(self, x):
            x = self.projection(x)
            out_size = (x.shape[2], x.shape[3])
            x = x.flatten(2).transpose(1, 2)
            if self.norm is not None:
                x = self.norm(x)
            return x, out_size

    def resize_pos_embed(pos_embed, src_shape, dst_shape, mode="bicubic", num_extra_tokens=1):
        if tuple(src_shape) == tuple(dst_shape):
            return pos_embed
        _, L, C = pos_embed.shape
        extra = pos_embed[:, :num_extra_tokens]
        grid = pos_embed[:, num_extra_tokens:]
        grid = grid.reshape(1, src_shape[0], src_shape[1], C).permute(0, 3, 1, 2)
        grid = F.interpolate(grid, size=dst_shape, mode=mode, align_corners=False)
        grid = grid.permute(0, 2, 3, 1).reshape(1, dst_shape[0] * dst_shape[1], C)
        return torch.cat([extra, grid], dim=1)

    class _Registry:
        def __init__(self, name="shim"): self.name, self._m = name, {}
        def register_module(self, *a, **k):
            def deco(cls):
                self._m[getattr(cls, "__name__", "x")] = cls
                return cls
            return deco(a[0]) if a and callable(a[0]) else deco
        def get(self, n): return self._m.get(n)
        def build(self, cfg, *a, **k):
            cfg = dict(cfg); cls = self._m[cfg.pop("type")]
            return cls(**cfg)

    exports = {
        "BaseModule": BaseModule, "PatchEmbed": PatchEmbed, "DropPath": DropPath,
        "trunc_normal_": trunc_normal_, "resize_pos_embed": resize_pos_embed,
        "BACKBONES": _Registry("BACKBONES"), "MODELS": _Registry("MODELS"),
        "ModuleList": nn.ModuleList, "Sequential": nn.Sequential,
        "build_norm_layer": lambda cfg, dims: ("norm", nn.LayerNorm(dims)),
        "build_dropout": lambda cfg: (DropPath(cfg.get("drop_prob", 0.0))
                                      if isinstance(cfg, dict) else nn.Identity()),
        "constant_init": lambda *a, **k: None, "get_root_logger": lambda *a, **k: None,
        "load_checkpoint": lambda *a, **k: None, "_load_checkpoint": lambda *a, **k: {},
    }

    class _ShimModule(types.ModuleType):
        def __getattr__(self, item):
            if item in exports:
                return exports[item]
            if item.startswith("__"):
                raise AttributeError(item)
            return type(item, (), {"__init__": lambda self, *a, **k: None})

    names = [
        "mmcv", "mmcv.cnn", "mmcv.cnn.bricks", "mmcv.cnn.bricks.transformer",
        "mmcv.cnn.bricks.drop", "mmcv.runner", "mmcv.runner.base_module", "mmcv.utils",
        "mmengine", "mmengine.model", "mmengine.logging", "mmengine.runner",
        "mmengine.registry", "mmengine.utils",
        "mmcls", "mmcls.models", "mmcls.models.builder", "mmcls.models.utils",
        "mmcls.models.backbones", "mmcls.models.backbones.base_backbone", "mmcls.utils",
        "mmpretrain", "mmpretrain.registry", "mmpretrain.models",
        "mmpretrain.models.utils", "mmpretrain.models.backbones",
        "mmseg", "mmseg.models", "mmseg.models.builder", "mmseg.utils", "mmseg.ops",
    ]
    for n in names:
        if n not in sys.modules:
            m = _ShimModule(n)
            for k, v in exports.items():
                setattr(m, k, v)
            sys.modules[n] = m
    # BaseBackbone is what mmcls backbones subclass
    sys.modules["mmcls.models.backbones.base_backbone"].BaseBackbone = BaseModule
    sys.modules["mmcls.models.backbones"].BaseBackbone = BaseModule
    return exports

class VRWKVFeatures(nn.Module):
    def __init__(self, backbone):
        super().__init__()
        self.backbone = backbone
    def forward(self, x):
        out = self.backbone(x)
        if isinstance(out, (tuple, list)):
            out = out[-1]
        if out.ndim == 4:
            out = out.mean(dim=(2, 3))
        elif out.ndim == 3:
            out = out.mean(dim=1)
        return out

_VRWKV_CLASS = None   # cached: the CUDA kernel is compiled only once per runtime

# The repository ships several vrwkv.py files. Only one of them is the backbone the
# official ImageNet-1k config instantiates (`type='VRWKV'` in
# configs/vrwkv/vrwkv_tiny_8xb128_in1k.py), and only that one's state_dict matches the
# released checkpoint. The others are the MAE-pretraining and detection/segmentation
# variants. Preference order is explicit rather than heuristic, because the MAE variant
# does `from vrwkv.utils import ...` and blows up with "'vrwkv' is not a package".
VRWKV_PREFERRED = [
    "classification/mmcls_custom/models/backbones/vrwkv.py",   # official in1k backbone
    "classification_internimage/models/vrwkv.py",
]

def _vrwkv_shim_drop_path(repo_root: Path) -> None:
    """Expose mmcls_custom.models.utils.DropPath without importing the real package.

    `mmcls_custom/__init__.py` does `from .models import *`, which re-imports vrwkv.py
    and would recurse. drop.py itself only needs torch.nn, so it is loaded directly.
    """
    import importlib.util as _ilu
    drop_py = repo_root / "classification/mmcls_custom/models/utils/drop.py"
    pkg_utils = types.ModuleType("mmcls_custom.models.utils")
    if drop_py.exists():
        spec = _ilu.spec_from_file_location("mmcls_custom_drop", drop_py)
        m = _ilu.module_from_spec(spec)
        spec.loader.exec_module(m)
        pkg_utils.DropPath = m.DropPath
    else:
        from timm.layers import DropPath as _DP
        pkg_utils.DropPath = _DP
    pkg_root = types.ModuleType("mmcls_custom")
    pkg_models = types.ModuleType("mmcls_custom.models")
    pkg_models.utils = pkg_utils
    pkg_root.models = pkg_models
    sys.modules.setdefault("mmcls_custom", pkg_root)
    sys.modules.setdefault("mmcls_custom.models", pkg_models)
    sys.modules["mmcls_custom.models.utils"] = pkg_utils

def _patch_cuda_arch(src_path: Path) -> Path:
    """Rewrite the hard-coded -gencode so the kernel is built for THIS GPU.

    The upstream file pins `arch=compute_86,code=sm_86`. `code=sm_86` emits SASS only,
    with no embedded PTX, so on any other architecture (an L4 is sm_89) there is no
    compatible cubin and nothing for the driver to JIT from. The edit is written to a
    copy so the clone stays pristine.
    """
    text = src_path.read_text()
    if "gencode" not in text:
        return src_path
    cc = torch.cuda.get_device_capability() if torch.cuda.is_available() else (8, 9)
    arch = f"{cc[0]}{cc[1]}"
    # keep PTX as well, so the kernel still runs if the GPU changes under us
    new_flag = (f"-gencode arch=compute_{arch},code=sm_{arch}', "
                f"'-gencode arch=compute_{arch},code=compute_{arch}")
    patched = re.sub(r"-gencode arch=compute_\d+,code=sm_\d+", new_flag, text)
    out = src_path.with_name("vrwkv_patched_arch.py")
    out.write_text(patched)
    print(f"    [vrwkv] CUDA arch retargeted to sm_{arch} (+PTX); upstream pinned sm_86")
    return out

CUDA_SOURCE_FIXES = [
    # THC was removed from PyTorch in 1.13/2.0. The kernel only uses plain atomicAdd
    # (a CUDA intrinsic), so the official successor header is a safe substitute.
    ("#include <THC/THCAtomics.cuh>", "#include <ATen/cuda/Atomic.cuh>"),
    # Tensor::type() is deprecated; AT_DISPATCH_* expects a ScalarType in modern torch.
    ('AT_DISPATCH_FLOATING_TYPES(k.type()', 'AT_DISPATCH_FLOATING_TYPES(k.scalar_type()'),
]

def _patch_cuda_sources(repo_root: Path) -> int:
    """Bring the upstream .cu/.cpp up to the torch 2.x API. Idempotent."""
    n = 0
    for path in (repo_root / "classification").rglob("*"):
        if path.suffix not in (".cu", ".cpp", ".cuh") or not path.is_file():
            continue
        text = path.read_text()
        new = text
        for old, rep in CUDA_SOURCE_FIXES:
            new = new.replace(old, rep)
        if new != text:
            path.write_text(new)
            n += 1
            print(f"    [vrwkv] torch-2.x API fixes applied to {path.name}")
    return n

def _load_with_log(spec, mod):
    """Execute the module, capturing the compiler output so a build failure is readable.

    torch.utils.cpp_extension.load() raises RuntimeError("Error building extension ...")
    with the actual nvcc/g++ diagnostics only on the captured stream. Without this the
    failure reports 22 seconds and nothing else.
    """
    buf = io.StringIO()
    try:
        with contextlib.redirect_stdout(buf), contextlib.redirect_stderr(buf):
            spec.loader.exec_module(mod)
    except Exception:
        log = buf.getvalue()
        errs = [ln for ln in log.splitlines()
                if any(t in ln.lower() for t in ("error", "fatal", "undefined", "no such file"))]
        print("    [vrwkv] --- compiler output (last 25 relevant lines) ---")
        for ln in (errs or log.splitlines())[-25:]:
            print(f"      {ln[:200]}")
        print("    [vrwkv] --- end compiler output ---")
        raise
    out = buf.getvalue()
    if out.strip():
        print(f"    [vrwkv] build finished ({len(out.splitlines())} log lines)")

def build_vision_rwkv(img_size: int):
    """Clone the official implementation, JIT-build its CUDA WKV op, load official weights."""
    global _VRWKV_CLASS
    repo_dir = Path("/content/Vision-RWKV")
    if not repo_dir.exists():
        r = subprocess.run(["git", "clone", "--depth", "1", VRWKV_REPO, str(repo_dir)],
                           capture_output=True, text=True)
        if r.returncode != 0:
            raise RuntimeError(f"git clone of the official Vision-RWKV repo failed: "
                               f"{r.stderr[-500:]}")

    if _VRWKV_CLASS is not None:
        return _finish_vrwkv(_VRWKV_CLASS, img_size)

    src = next((repo_dir / rel for rel in VRWKV_PREFERRED if (repo_dir / rel).exists()), None)
    if src is None:
        raise RuntimeError(
            "None of the expected Vision-RWKV backbone files were found in the clone: "
            f"{VRWKV_PREFERRED}. The upstream repository layout has changed; Vision-RWKV "
            "is reported as FAILED rather than guessed at.")
    # The official load() uses paths relative to `classification/`, e.g.
    # "mmcls_custom/models/backbones/cuda_new/bi_wkv.cpp".
    run_root = repo_dir / "classification"
    print(f"    [vrwkv] backbone source : {src.relative_to(repo_dir)}")

    _install_mm_shims()
    _vrwkv_shim_drop_path(repo_dir)
    _patch_cuda_sources(repo_dir)
    src = _patch_cuda_arch(src)

    import importlib.util
    cwd = os.getcwd()
    try:
        os.chdir(run_root)
        sys.path.insert(0, str(run_root))
        spec = importlib.util.spec_from_file_location("official_vrwkv", src)
        mod = importlib.util.module_from_spec(spec)
        sys.modules["official_vrwkv"] = mod
        _load_with_log(spec, mod)             # <- compiles the CUDA kernel (2-5 min, once)
    finally:
        os.chdir(cwd)

    VRWKV = getattr(mod, "VRWKV", None) or getattr(mod, "VRWKV_Net", None)
    if VRWKV is None:
        raise RuntimeError(f"No VRWKV class exported by {src}")
    _VRWKV_CLASS = VRWKV
    return _finish_vrwkv(VRWKV, img_size)

def _finish_vrwkv(VRWKV, img_size: int):
    # Official VRWKV-T geometry (Duan et al., 2024): 192 dims, 12 layers, patch 16.
    # drop_path_rate comes from CFG so that stochastic depth is identical for every
    # architecture. Hard-coding 0.1 here (v1) regularised Vision-RWKV alone.
    tiny = dict(img_size=img_size, patch_size=16, embed_dims=192, depth=12,
                drop_path_rate=CFG.drop_path_rate, in_channels=3)
    import inspect
    sig = inspect.signature(VRWKV.__init__).parameters
    alias = {"embed_dims": ["embed_dims", "embed_dim"], "depth": ["depth", "num_layers", "depths"],
             "img_size": ["img_size"], "patch_size": ["patch_size"],
             "drop_path_rate": ["drop_path_rate"], "in_channels": ["in_channels", "in_chans"]}
    kwargs = {}
    for key, val in tiny.items():
        for a in alias[key]:
            if a in sig:
                kwargs[a] = val
                break
    backbone = VRWKV(**kwargs)

    # ---- official pretrained checkpoint -------------------------------------
    from huggingface_hub import list_repo_files, hf_hub_download
    ckpt = None
    try:
        files = list_repo_files(VRWKV_HF, token=HF_TOKEN)
        cand = [f for f in files if f.endswith(".pth")
                and re.search(r"(tiny|_t_|-t-|vrwkv_t)", f, re.I)
                and re.search(r"(in1k|cls|1k|224)", f, re.I)]
        cand = cand or [f for f in files if f.endswith(".pth") and re.search(r"(tiny|_t_)", f, re.I)]
        if cand:
            ckpt = hf_hub_download(VRWKV_HF, sorted(cand, key=len)[0], token=HF_TOKEN)
    except Exception as e:  # noqa: BLE001
        print(f"    [vrwkv] HF checkpoint lookup failed: {type(e).__name__}: {e}")
    if ckpt is None:
        raise RuntimeError(
            "Official Vision-RWKV-T ImageNet weights could not be downloaded from "
            f"'{VRWKV_HF}'. Training from random initialisation would violate the study protocol, "
            "so Vision-RWKV is reported as FAILED rather than run un-pretrained.")

    sd = torch.load(ckpt, map_location="cpu", weights_only=False)
    for k in ("state_dict", "model", "module"):
        if isinstance(sd, dict) and k in sd:
            sd = sd[k]
    sd = {re.sub(r"^(backbone\.|module\.)", "", k): v for k, v in sd.items()}
    missing, unexpected = backbone.load_state_dict(sd, strict=False)
    matched = len(backbone.state_dict()) - len(missing)
    print(f"    [vrwkv] checkpoint {Path(ckpt).name}: {matched}/{len(backbone.state_dict())} "
          f"tensors matched, {len(missing)} missing, {len(unexpected)} unexpected")
    if matched < 0.6 * len(backbone.state_dict()):
        raise RuntimeError(
            f"Only {matched}/{len(backbone.state_dict())} Vision-RWKV tensors matched the official "
            "checkpoint. The backbone would be mostly randomly initialised, so it is reported as "
            "FAILED rather than silently benchmarked.")
    return (VRWKVFeatures(backbone), "Vision-RWKV-T",
            f"{VRWKV_HF}:{Path(ckpt).name}", IMAGENET_MEAN, IMAGENET_STD, False)

# ------------------------------------------------------------------ registry --
MODEL_BUILDERS = OrderedDict([
    ("dinov3_vits16",   build_dinov3),
    ("convnextv2_tiny", build_convnextv2),
    ("mambavision_t",   build_mambavision),
    ("vrwkv_t",         build_vision_rwkv),
])
MODEL_FAMILY = {
    "dinov3_vits16":   "Self-supervised ViT (foundation model)",
    "convnextv2_tiny": "Modern CNN",
    "mambavision_t":   "State-space / Transformer hybrid",
    "vrwkv_t":         "Linear-recurrent (RWKV) ViT",
}
print(f"{len(MODEL_BUILDERS)} builders registered: {list(MODEL_BUILDERS)}")

# ==========================================================================
# v3 ADDITION - five further backbones
# ==========================================================================
# Two of the four v1 architectures failed their compatibility check, leaving a
# two-model comparison. The paper's central claim is that the *evaluation
# protocol* moves reported performance by more than the architecture does, and
# that the size of that movement is itself architecture-dependent. Testing that
# claim needs more than two architectures.
#
# Every addition below is a plain timm checkpoint with no CUDA extension, so
# none of them can fail the way MambaVision and Vision-RWKV did. MambaVision and
# Vision-RWKV are deliberately left in the registry: they still run, still fail,
# and are still reported as EXCLUDED with their exact dependency error.

class TimmFeaturesSafe(nn.Module):
    """Pool a timm backbone to [B, D] for NCHW, NHWC and token layouts.

    `TimmFeatures` averages dims (2, 3). That is correct for NCHW feature maps but
    silently wrong for the channels-last maps some hierarchical backbones return,
    where it would average over width and channels. The expected width is read
    from `model.num_features`, the pooling axis is chosen to match it, and the
    result is asserted on the first forward pass.
    """
    def __init__(self, model):
        super().__init__()
        self.model = model
        self.width = int(getattr(model, "num_features", 0))
        self._checked = False

    def forward(self, x):
        f = self.model(x)
        if f.ndim == 4:
            f = f.mean(dim=(2, 3)) if f.shape[1] == self.width else f.mean(dim=(1, 2))
        elif f.ndim == 3:
            f = f.mean(dim=1)
        if not self._checked:
            if self.width and f.shape[1] != self.width:
                raise RuntimeError(
                    f"pooled width {f.shape[1]} != model.num_features {self.width}: "
                    "the pooling axis is wrong and the features would be scrambled.")
            self._checked = True
        return f


class PrefixPatchConcatFeatures(DinoV3Features):
    """CLS concatenated with the patch-token mean, for any timm ViT.

    DINOv3 is pooled as concat(CLS, mean(patch tokens)) -> 2 x width = 768. If
    DeiT III ViT-S/16 - the matched-capacity *supervised* control - were pooled as
    CLS only, the two ViT-S/16 models would differ in head input width (384 vs
    768) as well as in pretraining regime, and the comparison would confound the
    two. It therefore gets identical pooling.
    """


def _timm_builder(name: str, display: str):
    """Factory for an ungated timm backbone with a uniform return signature.

    Normalisation constants come from the checkpoint's own `default_cfg`, exactly
    as for ConvNeXt V2. Some checkpoints (the `tf_` EfficientNetV2 line) were
    pretrained with (0.5, 0.5, 0.5) rather than ImageNet statistics. Using the
    official values is a property of the released weights rather than a tuning
    knob; the compatibility check prints the resulting set, and any difference
    must be stated in Section 7.1 of the manuscript.
    """
    def _build(img_size: int):
        kw = dict(pretrained=True, num_classes=0)
        try:                                   # stochastic depth held identical
            m = timm.create_model(name, drop_path_rate=CFG.drop_path_rate, **kw)
        except TypeError:                      # backbone exposes no drop-path arg
            m = timm.create_model(name, **kw)
        dcfg = m.default_cfg
        return (TimmFeaturesSafe(m), display, f"timm:{name}",
                tuple(dcfg.get("mean", IMAGENET_MEAN)),
                tuple(dcfg.get("std", IMAGENET_STD)), False)
    return _build


def build_deit3_small(img_size: int):
    """DeiT III ViT-S/16, IN-22k pretrained + IN-1k fine-tuned.

    This is the scientifically important addition: same architecture, same patch
    size and same capacity as DINOv3 ViT-S/16, but supervised rather than
    self-supervised pretraining. It isolates the pretraining regime from the
    backbone, which the DINOv3-vs-ConvNeXt comparison cannot do.
    """
    name = "deit3_small_patch16_224.fb_in22k_ft_in1k"
    m = timm.create_model(name, pretrained=True, num_classes=0,
                          img_size=img_size, drop_path_rate=CFG.drop_path_rate)
    dcfg = m.default_cfg
    return (PrefixPatchConcatFeatures(m, patch_size=16), "DeiT III ViT-S/16",
            f"timm:{name}", tuple(dcfg.get("mean", IMAGENET_MEAN)),
            tuple(dcfg.get("std", IMAGENET_STD)), False)


# key -> (builder, display, family). Trim ENABLE_EXTRA if the budget is tight:
# each entry costs roughly 1.0-1.5 GPU-hours for 5 seeds in Section 9.2, and the
# same again for the Section 18 protocol ablation.
EXTRA_BACKBONES = OrderedDict([
    ("deit3_small",  (build_deit3_small,
                      "DeiT III ViT-S/16", "Supervised ViT")),
    ("swin_tiny",    (_timm_builder("swin_tiny_patch4_window7_224.ms_in1k", "Swin-T"),
                      "Swin-T", "Hierarchical windowed ViT")),
    ("resnet50",     (_timm_builder("resnet50.a1_in1k", "ResNet-50"),
                      "ResNet-50", "Classic CNN")),
    ("effnetv2_s",   (_timm_builder("tf_efficientnetv2_s.in21k_ft_in1k", "EfficientNetV2-S"),
                      "EfficientNetV2-S", "Efficiency-oriented CNN")),
    ("densenet121",  (_timm_builder("densenet121.ra_in1k", "DenseNet-121"),
                      "DenseNet-121", "Classic CNN")),
])

ENABLE_EXTRA = ("deit3_small", "swin_tiny", "resnet50", "effnetv2_s", "densenet121")

for _k in ENABLE_EXTRA:
    _builder, _display, _family = EXTRA_BACKBONES[_k]
    MODEL_BUILDERS[_k] = _builder
    MODEL_FAMILY[_k] = _family

print(f"v3: {len(ENABLE_EXTRA)} extra backbones registered -> "
      f"{len(MODEL_BUILDERS)} builders total: {list(MODEL_BUILDERS)}")
print("     ResNet-50 and DenseNet-121 are included as literature anchors: they are")
print("     the backbones most published HAM10000 results are built on, so they let")
print("     this study's numbers be read against that literature directly.")


4 builders registered: ['dinov3_vits16', 'convnextv2_tiny', 'mambavision_t', 'vrwkv_t']
v3: 5 extra backbones registered -> 9 builders total: ['dinov3_vits16', 'convnextv2_tiny', 'mambavision_t', 'vrwkv_t', 'deit3_small', 'swin_tiny', 'resnet50', 'effnetv2_s', 'densenet121']
     ResNet-50 and DenseNet-121 are included as literature anchors: they are
     the backbones most published HAM10000 results are built on, so they let
     this study's numbers be read against that literature directly.


### 7.5 Compatibility Check

Before a single GPU-hour is spent, every architecture is instantiated, moved to the GPU, and run
forward **and backward** on a dummy `(2, 3, 224, 224)` tensor. This catches missing CUDA
extensions, gated-repo errors, dtype problems, and shape mismatches in seconds instead of after
an hour of training.

The result of this cell determines `AVAILABLE_MODELS`. Models that fail are excluded from the
study and are reported as `EXCLUDED` in Tables 3-7 and in the final summary — they are never
quietly replaced.

In [ ]:
# ============================================================================
# Cell 7.4 - Compatibility check on a dummy 224x224 tensor
# ============================================================================
MODEL_INFO: dict[str, dict] = {}
COMPAT_ROWS = []

def probe_drop_path(module) -> float:
    """Largest stochastic-depth probability actually present in a backbone."""
    vals = [float(getattr(m, "drop_prob", 0.0)) for m in module.modules()
            if "droppath" in type(m).__name__.lower()]
    return max(vals) if vals else 0.0

print("=" * 96)
print(f"COMPATIBILITY CHECK - dummy input (2, 3, {CFG.img_size}, {CFG.img_size})")
print("=" * 96)

for key, builder in MODEL_BUILDERS.items():
    print(f"\n>>> {key}")
    row = {"key": key, "family": MODEL_FAMILY[key], "display": key,
           "source": "-", "feat_dim": None, "params_M": None,
           "fwd_bwd_ok": False, "status": "FAILED", "note": ""}
    t0 = time.perf_counter()
    try:
        backbone, display, source, mean, std, is_fallback = builder(CFG.img_size)
        feat_dim = infer_feature_dim(backbone, CFG.img_size, DEVICE)
        model = LesionClassifier(backbone, feat_dim, NUM_CLASSES).to(DEVICE)
        x = torch.randn(2, 3, CFG.img_size, CFG.img_size, device=DEVICE)
        model.train()
        with torch.autocast("cuda", dtype=AMP_DTYPE, enabled=CFG.amp):
            y = model(x)
            loss = y.float().square().mean()
        loss.backward()
        assert y.shape == (2, NUM_CLASSES), f"bad output shape {tuple(y.shape)}"
        n_par = sum(p.numel() for p in model.parameters())
        MODEL_INFO[key] = {"display": display, "source": source, "family": MODEL_FAMILY[key],
                           "feat_dim": feat_dim, "mean": mean, "std": std,
                           "is_fallback": is_fallback, "params_total": n_par}
        dp = probe_drop_path(model.backbone)
        MODEL_INFO[key]["drop_path"] = dp
        MODEL_INFO[key]["norm_mean"] = tuple(round(float(v), 4) for v in mean)
        MODEL_INFO[key]["norm_std"] = tuple(round(float(v), 4) for v in std)
        row.update(display=display, source=source, feat_dim=feat_dim,
                   params_M=n_par / 1e6, fwd_bwd_ok=True, status="OK",
                   drop_path=dp, norm_mean=str(MODEL_INFO[key]["norm_mean"]),
                   norm_std=str(MODEL_INFO[key]["norm_std"]),
                   note="DOCUMENTED FALLBACK - not the requested architecture" if is_fallback else "")
        print(f"    OK  | {display} | feat_dim={feat_dim} | {n_par / 1e6:.2f} M params "
              f"| build {time.perf_counter() - t0:.1f}s")
        if is_fallback:
            print("    !!! this is a DOCUMENTED FALLBACK and is labelled as such in every table")
        del model, backbone, x, y, loss
        gc.collect(); torch.cuda.empty_cache()
    except Exception as e:  # noqa: BLE001
        row["note"] = f"{type(e).__name__}: {e}"
        print(f"    FAILED after {time.perf_counter() - t0:.1f}s")
        for line in str(e).splitlines()[:8]:
            print("      " + line)
    COMPAT_ROWS.append(row)

compat_df = pd.DataFrame(COMPAT_ROWS).reindex(
    columns=["key", "display", "family", "status", "feat_dim", "params_M",
             "drop_path", "norm_mean", "norm_std", "source", "note"])

# ---- input-side fairness: every model must see identically preprocessed pixels ----
_ok = [r for r in COMPAT_ROWS if r["status"] == "OK"]
if _ok:
    _norms = {(r.get("norm_mean"), r.get("norm_std")) for r in _ok}
    _dps = {r.get("drop_path", 0.0) for r in _ok}
    print(f"\nInput normalisation in force: {_norms}")
    if len(_norms) > 1:
        print("  NOTE: models use different normalisation constants. This is correct only if")
        print("  each set is the official preprocessing for that checkpoint - state it explicitly.")
    else:
        print("  All models share identical normalisation constants.")
    print(f"Stochastic depth in force   : {_dps}"
          f"{'  <- IDENTICAL' if len(_dps) == 1 else '  <- DIFFERS, see fairness audit'}")
save_table(compat_df, "table_compatibility_check", "Compatibility check")

AVAILABLE_MODELS = [r["key"] for r in COMPAT_ROWS if r["status"] == "OK"]
EXCLUDED_MODELS = {r["key"]: r["note"] for r in COMPAT_ROWS if r["status"] != "OK"}

print("\n" + "=" * 96)
print(compat_df.drop(columns=["note"]).to_string(index=False,
      float_format=lambda v: f"{v:.2f}"))
print("=" * 96)
print(f"AVAILABLE : {AVAILABLE_MODELS}")
if EXCLUDED_MODELS:
    print(f"EXCLUDED  : {list(EXCLUDED_MODELS)}")
    print("  These architectures are NOT replaced. Every downstream table will show them as")
    print("  EXCLUDED together with the exact dependency error above.")
if not AVAILABLE_MODELS:
    raise RuntimeError("No architecture could be built - fix the dependency errors above.")
if len(AVAILABLE_MODELS) < 2:
    print("\nWARNING: fewer than two models are available; Section 12 (pairwise statistical "
          "testing) will have nothing to compare.")

COMPATIBILITY CHECK - dummy input (2, 3, 224, 224)

>>> dinov3_vits16


model.safetensors: reconstructing file:   0%|          |  0.00B / 86.4MB            

model.safetensors: downloading bytes:           |  0.00B            

    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
    OK  | DINOv3 ViT-S/16 | feat_dim=768 | 21.59 M params | build 4.7s

>>> convnextv2_tiny


model.safetensors: reconstructing file:   0%|          |  0.00B /  115MB            

...

model.safetensors: downloading bytes:           |  0.00B            

    OK  | EfficientNetV2-S | feat_dim=1280 | 20.19 M params | build 2.9s

>>> densenet121


model.safetensors: reconstructing file:   0%|          |  0.00B / 32.3MB            

model.safetensors: downloading bytes:           |  0.00B            

    OK  | DenseNet-121 | feat_dim=1024 | 6.96 M params | build 1.7s

Input normalisation in force: {('(0.5, 0.5, 0.5)', '(0.5, 0.5, 0.5)'), ('(0.485, 0.456, 0.406)', '(0.229, 0.224, 0.225)')}
  NOTE: models use different normalisation constants. This is correct only if
  each set is the official preprocessing for that checkpoint - state it explicitly.
Stochastic depth in force   : {0.0}  <- IDENTICAL

            key           display                                 family status  feat_dim  params_M  drop_path             norm_mean              norm_std                                        source
  dinov3_vits16   DINOv3 ViT-S/16 Self-supervised ViT (foundation model)     OK    768.00     21.59       0.00 (0.485, 0.456, 0.406) (0.229, 0.224, 0.225)        timm:vit_small_patch16_dinov3.lvd1689m
convnextv2_tiny  ConvNeXt V2-Tiny                             Modern CNN     OK    768.00     27.87       0.00 (0.485, 0.456, 0.406) (0.229, 0.224, 0.225)      timm:convnextv2_tiny.fcmae_ft_in2

In [ ]:
# ============================================================================
# Cell 7.5 - GATE A: model integrity and input-side fairness
# ============================================================================
# Everything expensive comes after this cell. These are exactly the conditions that
# would invalidate the benchmark rather than merely degrade it.
print("=" * 78)
print("GATE A - model integrity (run before committing any GPU time)")
print("=" * 78)

_ok_rows = [r for r in COMPAT_ROWS if r["status"] == "OK"]
gate("at least two models instantiate", len(_ok_rows) >= 2,
     f"{len(_ok_rows)}/{len(MODEL_BUILDERS)} available",
     "A pairwise comparison needs two models. Fix the dependency errors printed above.")

_missing = [k for k in MODEL_BUILDERS if k not in AVAILABLE_MODELS]
if _missing:
    print(f"  NOTE: excluded - {', '.join(MODEL_INFO.get(k, {}).get('display', k) for k in _missing)}")
    print("        They will appear as EXCLUDED in every table with their exact exception.")
    print("        Nothing is substituted. Decide now whether to proceed without them.")

_fb = [k for k in AVAILABLE_MODELS if MODEL_INFO[k].get("is_fallback")]
gate("no unintended fallback backbone", not _fb,
     f"fallback in use: {_fb}" if _fb else "all backbones are the intended checkpoints",
     "ALLOW_DINOV3_FALLBACK is on. If that is deliberate, set STOP_ON_GATE_FAILURE = False; "
     "the model is already relabelled [FALLBACK] everywhere.")

_dps = {round(MODEL_INFO[k].get("drop_path", 0.0), 6) for k in AVAILABLE_MODELS}
gate("stochastic depth identical across models", len(_dps) == 1,
     f"drop-path values in force: {sorted(_dps)}",
     "One model is regularised differently from the others, which confounds the comparison. "
     "Check CFG.drop_path_rate and the builder for the outlier.")

_norms = {(MODEL_INFO[k].get("norm_mean"), MODEL_INFO[k].get("norm_std"))
          for k in AVAILABLE_MODELS}
if len(_norms) == 1:
    gate("input normalisation identical across models", True,
         f"{next(iter(_norms))[0]} / {next(iter(_norms))[1]}")
else:
    print("  [WARN] models use different normalisation constants.")
    print("         This is defensible only if each set is the official preprocessing for that")
    print("         checkpoint - if so, state it explicitly in the write-up and continue.")
    for k in AVAILABLE_MODELS:
        print(f"         {MODEL_INFO[k]['display']:<26} {MODEL_INFO[k].get('norm_mean')} "
              f"{MODEL_INFO[k].get('norm_std')}")

gate("feature dimension probed for every model",
     all(MODEL_INFO[k].get("feat_dim", 0) > 0 for k in AVAILABLE_MODELS),
     ", ".join(f"{MODEL_INFO[k]['display']}={MODEL_INFO[k]['feat_dim']}"
               for k in AVAILABLE_MODELS))

_fails = [k for k, v in AUDIT.items() if v["status"] == "FAIL"]
_infos = [k for k, v in AUDIT.items() if v["status"] == "INFO"]
gate("no blocking leakage failure", not _fails,
     f"{len(AUDIT) - len(_fails) - len(_infos)} passed, {len(_infos)} informational, "
     f"{len(_fails)} failed"
     + ("" if not _fails else "; failing: " + ", ".join(_fails)),
     "Section 5/6 reported a blocking FAIL. Fix the split before training anything.")
if _infos:
    print("        informational (observed, not blocking): " + ", ".join(_infos))

print("\nGate A passed. Proceed to Stage 5a (Sections 8.1-9.2a).")


GATE A - model integrity (run before committing any GPU time)
  [PASS] at least two models instantiate  -- 7/9 available
  NOTE: excluded - mambavision_t, vrwkv_t
        They will appear as EXCLUDED in every table with their exact exception.
        Nothing is substituted. Decide now whether to proceed without them.
  [PASS] no unintended fallback backbone  -- all backbones are the intended checkpoints
  [PASS] stochastic depth identical across models  -- drop-path values in force: [0.0]
  [WARN] models use different normalisation constants.
         This is defensible only if each set is the official preprocessing for that
         checkpoint - if so, state it explicitly in the write-up and continue.
         DINOv3 ViT-S/16            (0.485, 0.456, 0.406) (0.229, 0.224, 0.225)
         ConvNeXt V2-Tiny           (0.485, 0.456, 0.406) (0.229, 0.224, 0.225)
         DeiT III ViT-S/16          (0.485, 0.456, 0.406) (0.229, 0.224, 0.225)
         Swin-T                     (0.485, 0.45

---
## 8. Training Configuration

### 8.1 Augmentation

Dermoscopic images have no canonical orientation, so the full dihedral group is admissible.
Augmentation is deliberately conservative: heavy colour distortion would destroy the pigment-network
and blue-white-veil cues that dermoscopic diagnosis depends on.

| Stage | Transform | Justification |
|---|---|---|
| train | `RandomResizedCrop(224, scale=(0.7, 1.0), ratio=(0.85, 1.18))` | scale invariance; the lower bound is kept high so the lesion is not cropped away |
| train | `RandomHorizontalFlip`, `RandomVerticalFlip` | orientation is arbitrary |
| train | `RandomRotation(20)` | rotation is arbitrary |
| train | `ColorJitter(0.15, 0.15, 0.10, 0.02)` | models mild illumination/white-balance variation between devices |
| val / test | `Resize(256) -> CenterCrop(224)` | **fully deterministic** — asserted in the leakage audit |

### 8.2 Class imbalance

We use **inverse-frequency class weighting** in `CrossEntropyLoss`, with weights computed on the
training split only: `w_c = N / (K · n_c)`, normalised to mean 1. Compared with the alternatives:

* *Oversampling* changes the number of gradient steps per epoch and would confound the
  "epochs" axis of the compute budget.
* *Focal loss* introduces a second hyperparameter (`gamma`) that would need tuning per
  architecture, which the budget does not allow and which would weaken the "identical recipe"
  control.

Weighted CE keeps the epoch definition, the step count, and the loss surface comparable across all
four architectures, which is what this study is actually measuring.

### 8.3 Two-stage schedule and learning rates

| | Stage 1 (linear probe) | Stage 2 (fine-tune) |
|---|---|---|
| epochs | 4 | up to 9 (early stopping, patience 3) |
| backbone | **frozen**, `eval()` mode | **fully unfrozen** |
| head LR | `1e-3` | `1e-4` |
| backbone LR | — | `1e-5` (ViT/RWKV) or `5e-5` (ConvNeXt/MambaVision) |
| schedule | cosine to 0 | 10 % linear warm-up, then cosine to 0 |

Stage 1 aligns a randomly initialised head before any gradient reaches the pretrained weights,
which prevents the large early gradients that otherwise erase pretrained features. In Stage 2 a
**discriminative learning rate** (backbone 10-100x lower than the head) is standard for transfer
learning; the lower value is used for the attention-based and recurrent backbones because
self-supervised and token-mixing representations are empirically more sensitive to disruption than
convolutional ones. `AdamW` with `weight_decay = 1e-4` (excluded from norms and biases) and
gradient clipping at 1.0 (stabilises the SSM/RWKV recurrences) complete the recipe.

**All four models receive the identical recipe.** No per-model tuning is performed, and the test
set is never consulted.

In [ ]:
# ============================================================================
# Cell 8.1 - Datasets, transforms, dataloaders
# ============================================================================
class LesionDataset(Dataset):
    def __init__(self, df: pd.DataFrame, transform, label_col: str = "label_idx"):
        self.paths = df["path"].tolist()
        self.labels = df[label_col].tolist() if label_col in df.columns else [0] * len(df)
        self.ids = df["image_id"].tolist()
        self.transform = transform
    def __len__(self):
        return len(self.paths)
    def __getitem__(self, i):
        with Image.open(self.paths[i]) as im:
            img = im.convert("RGB")
        return self.transform(img), int(self.labels[i]), i

def build_transforms(mean, std, img_size: int):
    train_tf = T.Compose([
        T.RandomResizedCrop(img_size, scale=(0.7, 1.0), ratio=(0.85, 1.18),
                            interpolation=T.InterpolationMode.BICUBIC),
        T.RandomHorizontalFlip(0.5),
        T.RandomVerticalFlip(0.5),
        T.RandomRotation(20, interpolation=T.InterpolationMode.BILINEAR),
        T.ColorJitter(brightness=0.15, contrast=0.15, saturation=0.10, hue=0.02),
        T.ToTensor(),
        T.Normalize(mean, std),
    ])
    eval_tf = T.Compose([
        T.Resize(int(img_size * 256 / 224), interpolation=T.InterpolationMode.BICUBIC),
        T.CenterCrop(img_size),
        T.ToTensor(),
        T.Normalize(mean, std),
    ])
    return train_tf, eval_tf

# --- augmentation-leakage check: evaluation transforms must be deterministic ---
_probe_train, _probe_eval = build_transforms(IMAGENET_MEAN, IMAGENET_STD, CFG.img_size)
_random_ops = [t.__class__.__name__ for t in _probe_eval.transforms
               if t.__class__.__name__.lower().startswith("random")]
record("no augmentation leakage into val/test", len(_random_ops) == 0,
       f"stochastic ops in eval pipeline: {_random_ops or 'none'}")
# this check can only run once build_transforms exists, so the audit table is refreshed here
save_table(pd.DataFrame([{"check": k, "status": v["status"], "detail": v["detail"]}
                         for k, v in AUDIT.items()]), "table_leakage_audit",
           "Data leakage audit (complete)")
if AUDIT["no augmentation leakage into val/test"]["status"] == "FAIL":
    raise RuntimeError("Stochastic transforms found in the evaluation pipeline - aborting.")

def make_loader(df, transform, batch_size, shuffle, seed, label_col="label_idx"):
    g = torch.Generator(); g.manual_seed(seed)
    return DataLoader(
        LesionDataset(df, transform, label_col), batch_size=batch_size, shuffle=shuffle,
        num_workers=CFG.num_workers, pin_memory=True, drop_last=False,
        persistent_workers=CFG.num_workers > 0,
        prefetch_factor=CFG.prefetch_factor if CFG.num_workers > 0 else None,
        worker_init_fn=seed_worker, generator=g)

# --- class weights from the TRAINING split only ------------------------------
counts = train_df.label_idx.value_counts().reindex(range(NUM_CLASSES)).fillna(0).values.astype(float)
class_weights = counts.sum() / (NUM_CLASSES * np.clip(counts, 1, None))
class_weights = class_weights / class_weights.mean()
CLASS_WEIGHTS = torch.tensor(class_weights, dtype=torch.float32, device=DEVICE)
print("Class weights (inverse frequency, train split only, mean-normalised):")
print(pd.DataFrame({"class": CLASSES, "train_n": counts.astype(int),
                    "weight": np.round(class_weights, 3)}).to_string(index=False))

  [PASS] no augmentation leakage into val/test      stochastic ops in eval pipeline: none
Class weights (inverse frequency, train split only, mean-normalised):
class  train_n  weight
akiec      253   0.817
  bcc      345   0.599
  bkl      768   0.269
   df       70   2.953
  mel      761   0.272
   nv     4711   0.044
 vasc      101   2.046


In [ ]:
# ============================================================================
# Cell 8.2 - Automatic batch-size selection (identical batch size for all models)
# ============================================================================
def max_batch_size(key: str, candidates=(64, 48, 32, 24, 16, 8)) -> int:
    """Largest batch that survives a full fwd+bwd+step for this backbone on this GPU."""
    info = MODEL_INFO[key]
    backbone, *_ = MODEL_BUILDERS[key](CFG.img_size)
    model = LesionClassifier(backbone, info["feat_dim"], NUM_CLASSES).to(DEVICE)
    opt = torch.optim.AdamW(model.parameters(), lr=1e-4)
    best = 0
    for bs in candidates:
        try:
            torch.cuda.empty_cache(); torch.cuda.reset_peak_memory_stats()
            x = torch.randn(bs, 3, CFG.img_size, CFG.img_size, device=DEVICE)
            y = torch.randint(0, NUM_CLASSES, (bs,), device=DEVICE)
            with torch.autocast("cuda", dtype=AMP_DTYPE, enabled=CFG.amp):
                loss = F.cross_entropy(model(x), y)
            loss.backward(); opt.step(); opt.zero_grad(set_to_none=True)
            best = bs
            print(f"    {key}: batch {bs:3d} OK  (peak {torch.cuda.max_memory_allocated()/1024**3:.2f} GiB)")
            break
        except torch.cuda.OutOfMemoryError:
            print(f"    {key}: batch {bs:3d} OOM")
            opt.zero_grad(set_to_none=True)
            gc.collect(); torch.cuda.empty_cache()
    del model, opt
    gc.collect(); torch.cuda.empty_cache()
    return best

# AMP_DTYPE / USE_SCALER were fixed in Section 2.5 so that the compatibility check
# in 7.4 exercised exactly the dtype used here.
print(f"Mixed precision: {AMP_DTYPE} | GradScaler={'yes' if USE_SCALER else 'no'}\n")

with Timer("batch_size_search", TIMINGS, verbose=False):
    per_model_bs = {k: max_batch_size(k) for k in AVAILABLE_MODELS} if torch.cuda.is_available() \
                   else {k: 8 for k in AVAILABLE_MODELS}
BATCH_SIZE = max(CFG.min_batch_size, min(CFG.max_batch_size, min(per_model_bs.values())))
print(f"\nPer-model maximum batch size: {per_model_bs}")
print(f"-> A SINGLE batch size of {BATCH_SIZE} is used for every model, so that optimisation "
      f"dynamics\n   (steps per epoch, effective LR, BN/LN statistics) are identical across "
      f"architectures.")
STEPS_PER_EPOCH = math.ceil(len(train_df) / BATCH_SIZE)
print(f"   Steps per epoch: {STEPS_PER_EPOCH}")

Mixed precision: torch.bfloat16 | GradScaler=no

    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
    dinov3_vits16: batch  64 OK  (peak 2.84 GiB)
    convnextv2_tiny: batch  64 OK  (peak 6.84 GiB)
    [dinov3] token layout verified: 1 prefix (1 CLS + 0 register) + 196 patch tokens, width 384 -> feature dim 768
    deit3_small: batch  64 OK  (peak 2.47 GiB)
    swin_tiny: batch  64 OK  (peak 4.41 GiB)
    resnet50: batch  64 OK  (peak 2.84 GiB)
    effnetv2_s: batch  64 OK  (peak 4.85 GiB)
    densenet121: batch  64 OK  (peak 4.08 GiB)

Per-model maximum batch size: {'dinov3_vits16': 64, 'convnextv2_tiny': 64, 'deit3_small': 64, 'swin_tiny': 64, 'resnet50': 64, 'effnetv2_s': 64, 'densenet121': 64}
-> A SINGLE batch size of 64 is used for every model, so that optimisation dynamics
   (steps per epoch, effective LR, BN/LN statistics) are identical across architectures.
   Steps per epoch: 110


In [ ]:
# ============================================================================
# Cell 8.3 - Table 2: training configuration
# ============================================================================
tab2 = pd.DataFrame([
    ("Input resolution",        f"{CFG.img_size} x {CFG.img_size}"),
    ("Batch size (all models)", str(BATCH_SIZE)),
    ("Steps per epoch",         str(STEPS_PER_EPOCH)),
    ("Stage 1 (frozen backbone)", f"{CFG.stage1_epochs} epochs, head LR {CFG.lr_head_stage1:g}, cosine"),
    ("Stage 2 (fine-tuning)",   f"<= {CFG.stage2_epochs} epochs, head LR {CFG.lr_head_stage2:g}, "
                                f"backbone LR selected per model on validation from "
                                f"{list(CFG.lr_grid)} (Section 9.2c), warm-up "
                                f"{CFG.warmup_frac:.0%} + cosine"),
    ("Optimiser",               f"AdamW (beta=0.9/0.999), weight decay {CFG.weight_decay:g} "
                                f"excluding norms and biases"),
    ("Loss",                    f"CrossEntropyLoss, inverse-frequency class weights, "
                                f"label smoothing {CFG.label_smoothing:g}"),
    ("Gradient clipping",       f"global norm {CFG.grad_clip:g}"),
    ("Mixed precision",         f"{AMP_DTYPE}".replace("torch.", "")),
    ("Early stopping",          f"validation macro-F1, patience {CFG.early_stopping_patience}, "
                                f"min delta {CFG.early_stopping_min_delta:g} (stage 2)"),
    ("Model selection",         "best validation macro-F1 checkpoint; test set never consulted"),
    ("Seeds",                   ", ".join(map(str, CFG.seeds))),
    ("Split",                   f"lesion-disjoint 70/15/15, split_seed {CFG.split_seed}, "
                                f"fingerprint {SPLIT_HASH}"),
    ("Hardware",                GPU_NAME),
], columns=["setting", "value"])
print("=" * 110)
print("TABLE 2 - Training configuration (identical for every architecture)")
print("=" * 110)
print(tab2.to_string(index=False))
save_table(tab2, "table2_training_configuration", "Table 2 - Training configuration")

TABLE 2 - Training configuration (identical for every architecture)
                  setting                                                                                                                                               value
         Input resolution                                                                                                                                           224 x 224
  Batch size (all models)                                                                                                                                                  64
          Steps per epoch                                                                                                                                                 110
Stage 1 (frozen backbone)                                                                                                                     4 epochs, head LR 0.001, cosine
    Stage 2 (fine-tuning) <= 16 epochs, head LR 0.0001, backbo

,setting,value
0,Input resolution,224 x 224
1,Batch size (all models),64
2,Steps per epoch,110
3,Stage 1 (frozen backbone),"4 epochs, head LR 0.001, cosine"
4,Stage 2 (fine-tuning),"<= 16 epochs, head LR 0.0001, backbone LR sele..."
5,Optimiser,"AdamW (beta=0.9/0.999), weight decay 0.0001 ex..."
6,Loss,"CrossEntropyLoss, inverse-frequency class weig..."
7,Gradient clipping,global norm 1
8,Mixed precision,bfloat16
9,Early stopping,"validation macro-F1, patience 3, min delta 0.0..."


---
## 9. Training

### 9.1 Metrics, checkpointing, and the run tracker

Model selection uses **validation macro-F1**, which weights every diagnostic class equally and is
therefore the appropriate selection criterion under this degree of imbalance. Checkpoints and
training history are written to `/content/checkpoints/` after every epoch, so a Colab disconnect
costs at most one epoch. `RunTracker` measures every epoch with `time.perf_counter()` and derives
the remaining-time estimate from the epochs that have actually completed — nothing is guessed.

In [ ]:
# ============================================================================
# Cell 9.1 - Metric computation
# ============================================================================
def compute_metrics(y_true, y_pred, probs=None, labels=None, class_names=None) -> dict:
    labels = list(range(NUM_CLASSES)) if labels is None else list(labels)
    class_names = class_names or [str(l) for l in labels]
    y_true, y_pred = np.asarray(y_true), np.asarray(y_pred)
    cm = confusion_matrix(y_true, y_pred, labels=labels)
    tp = np.diag(cm).astype(float)
    fp = cm.sum(0) - tp
    fn = cm.sum(1) - tp
    tn = cm.sum() - tp - fp - fn
    sens = tp / np.clip(tp + fn, 1, None)
    spec = tn / np.clip(tn + fp, 1, None)
    m = {
        "accuracy": accuracy_score(y_true, y_pred),
        "balanced_accuracy": balanced_accuracy_score(y_true, y_pred),
        "macro_precision": precision_score(y_true, y_pred, labels=labels, average="macro", zero_division=0),
        "macro_recall": recall_score(y_true, y_pred, labels=labels, average="macro", zero_division=0),
        "macro_f1": f1_score(y_true, y_pred, labels=labels, average="macro", zero_division=0),
        "weighted_f1": f1_score(y_true, y_pred, labels=labels, average="weighted", zero_division=0),
        "n": int(len(y_true)),
    }
    per_class_f1 = f1_score(y_true, y_pred, labels=labels, average=None, zero_division=0)
    per_class_prec = precision_score(y_true, y_pred, labels=labels, average=None,
                                     zero_division=0)
    for i, c in enumerate(class_names):
        m[f"f1_{c}"] = float(per_class_f1[i])
        m[f"precision_{c}"] = float(per_class_prec[i])
        m[f"sensitivity_{c}"] = float(sens[i])
        m[f"specificity_{c}"] = float(spec[i])
    # ROC-AUC only where it is statistically defined (every class must be present)
    if probs is not None:
        probs = np.asarray(probs)
        present = set(np.unique(y_true))
        try:
            if probs.ndim == 1 or probs.shape[1] == 1:
                m["roc_auc"] = roc_auc_score(y_true, probs.ravel()) if len(present) == 2 else np.nan
            elif len(present) == len(labels):
                m["roc_auc_macro_ovr"] = roc_auc_score(y_true, probs, multi_class="ovr",
                                                       average="macro", labels=labels)
                m["roc_auc_weighted_ovr"] = roc_auc_score(y_true, probs, multi_class="ovr",
                                                          average="weighted", labels=labels)
            else:
                m["roc_auc_macro_ovr"] = np.nan
                m["roc_auc_note"] = f"undefined: only {len(present)}/{len(labels)} classes present"
        except Exception as e:  # noqa: BLE001
            m["roc_auc_macro_ovr"] = np.nan
            m["roc_auc_note"] = f"undefined ({type(e).__name__})"
    m["confusion_matrix"] = cm.tolist()
    return m

In [ ]:
# ============================================================================
# Cell 9.2 - Train / evaluate loops, early stopping, run tracker
# ============================================================================
class RunTracker:
    """Measures every epoch and derives an ETA from completed epochs only."""
    def __init__(self, planned_runs: int, epochs_per_run: int):
        self.planned_epochs = planned_runs * epochs_per_run
        self.epoch_times: list[float] = []
        self.run_times: dict[str, float] = {}
        self.t0 = time.perf_counter()
    def log_epoch(self, seconds: float) -> None:
        self.epoch_times.append(seconds)
    def log_run(self, name: str, seconds: float) -> None:
        self.run_times[name] = seconds
    @property
    def mean_epoch(self) -> float:
        return float(np.mean(self.epoch_times)) if self.epoch_times else float("nan")
    def eta_string(self) -> str:
        if not self.epoch_times:
            return "n/a (no epoch completed yet)"
        remaining = max(self.planned_epochs - len(self.epoch_times), 0)
        secs = remaining * self.mean_epoch
        return (f"{fmt_hms(secs)} (upper bound: {remaining} epochs x "
                f"{self.mean_epoch:.1f}s mean; early stopping can only reduce this)")

@torch.no_grad()
def evaluate(model, loader, criterion=None, return_probs=False):
    model.eval()
    logits_all, y_all, loss_sum, n = [], [], 0.0, 0
    for x, y, _ in loader:
        x = x.to(DEVICE, non_blocking=True)
        y = y.to(DEVICE, non_blocking=True)
        with torch.autocast("cuda", dtype=AMP_DTYPE, enabled=CFG.amp):
            out = model(x)
        if criterion is not None:
            loss_sum += criterion(out.float(), y).item() * y.size(0)
        n += y.size(0)
        logits_all.append(out.float().cpu())
        y_all.append(y.cpu())
    logits = torch.cat(logits_all)
    y_true = torch.cat(y_all).numpy()
    probs = torch.softmax(logits, dim=1).numpy()
    preds = probs.argmax(1)
    out = {"loss": loss_sum / max(n, 1), "y_true": y_true, "y_pred": preds}
    if return_probs:
        out["probs"] = probs
        out["logits"] = logits.numpy()
    return out

def train_one_epoch(model, loader, criterion, optimizer, scheduler, scaler):
    model.train()
    if not any(p.requires_grad for p in model.backbone.parameters()):
        model.backbone.eval()          # keep frozen BN/LN statistics fixed in stage 1
    total, correct, loss_sum = 0, 0, 0.0
    for x, y, _ in tqdm(loader, leave=False, desc="train"):
        x = x.to(DEVICE, non_blocking=True)
        y = y.to(DEVICE, non_blocking=True)
        optimizer.zero_grad(set_to_none=True)
        with torch.autocast("cuda", dtype=AMP_DTYPE, enabled=CFG.amp):
            out = model(x)
            loss = criterion(out.float(), y)
        if scaler is not None:
            scaler.scale(loss).backward()
            scaler.unscale_(optimizer)
            torch.nn.utils.clip_grad_norm_(model.parameters(), CFG.grad_clip)
            scaler.step(optimizer); scaler.update()
        else:
            loss.backward()
            torch.nn.utils.clip_grad_norm_(model.parameters(), CFG.grad_clip)
            optimizer.step()
        if scheduler is not None:
            scheduler.step()
        loss_sum += loss.item() * y.size(0)
        correct += (out.argmax(1) == y).sum().item()
        total += y.size(0)
    return loss_sum / max(total, 1), correct / max(total, 1)

def cosine_with_warmup(optimizer, total_steps: int, warmup_steps: int):
    def fn(step):
        if step < warmup_steps:
            return (step + 1) / max(warmup_steps, 1)
        prog = (step - warmup_steps) / max(total_steps - warmup_steps, 1)
        return 0.5 * (1 + math.cos(math.pi * min(prog, 1.0)))
    return torch.optim.lr_scheduler.LambdaLR(optimizer, fn)

def make_protocol(train, val, test, split_hash: str, name: str, suffix: str = "") -> dict:
    """Bundle everything that a split determines, so a protocol can be swapped wholesale.

    Class weights and steps-per-epoch are recomputed from the supplied training split using
    exactly the rule in Section 8.1 - they are properties of the protocol, not constants.
    """
    counts = (train.label_idx.value_counts().reindex(range(NUM_CLASSES))
              .fillna(0).values.astype(float))
    w = counts.sum() / (NUM_CLASSES * np.clip(counts, 1, None))
    w = w / w.mean()
    return {"train": train, "val": val, "test": test, "split_hash": split_hash,
            "name": name, "suffix": suffix, "weights_np": w,
            "weights_t": torch.tensor(w, dtype=torch.float32, device=DEVICE),
            "steps_per_epoch": math.ceil(len(train) / BATCH_SIZE)}

def default_protocol() -> dict:
    """The lesion-disjoint protocol of Section 6, reusing the already-computed weights."""
    p = make_protocol(train_df, val_df, test_df, SPLIT_HASH, "lesion-disjoint", "")
    p["weights_np"], p["weights_t"] = class_weights, CLASS_WEIGHTS
    p["steps_per_epoch"] = STEPS_PER_EPOCH
    return p

def run_experiment(key: str, seed: int, tracker: RunTracker, protocol=None) -> dict:
    # `protocol` is the ONLY thing that differs between the main benchmark and the
    # leakage ablation in Section 18. Everything below is shared code, so the measured
    # difference cannot be an artefact of two separate training implementations.
    proto = protocol if protocol is not None else default_protocol()
    tr_df, va_df = proto["train"], proto["val"]
    steps_per_epoch = proto["steps_per_epoch"]
    info = MODEL_INFO[key]
    run_id = f"{key}_seed{seed}{proto['suffix']}"
    ckpt_dir = CFG.ckpt_dir / run_id
    ckpt_dir.mkdir(parents=True, exist_ok=True)

    set_all_seeds(seed)
    train_tf, eval_tf = build_transforms(info["mean"], info["std"], CFG.img_size)
    train_loader = make_loader(tr_df, train_tf, BATCH_SIZE, True, seed)
    val_loader   = make_loader(va_df, eval_tf,  BATCH_SIZE * 2, False, seed)

    backbone, *_ = MODEL_BUILDERS[key](CFG.img_size)
    model = LesionClassifier(backbone, info["feat_dim"], NUM_CLASSES).to(DEVICE)
    criterion = nn.CrossEntropyLoss(weight=proto["weights_t"],
                                    label_smoothing=CFG.label_smoothing)
    lr_backbone = BACKBONE_LR[key]        # selected on validation in Section 9.2c

    print("\n" + "=" * 84)
    print("EXPERIMENT")
    print(f"  Model        : {info['display']}   [{info['family']}]")
    print(f"  Weights      : {info['source']}")
    print(f"  Seed         : {seed}")
    print(f"  GPU          : {GPU_NAME}")
    print(f"  Image size   : {CFG.img_size}")
    print(f"  Epochs       : {CFG.total_epochs} ({CFG.stage1_epochs} frozen + {CFG.stage2_epochs} FT)")
    print(f"  Batch size   : {BATCH_SIZE}")
    print(f"  LR           : head {CFG.lr_head_stage1:g}/{CFG.lr_head_stage2:g} | "
          f"backbone {lr_backbone:g}")
    print(f"  Protocol     : {proto['name']}")
    print(f"  Split        : {proto['split_hash']}  (train {len(tr_df)} / val {len(va_df)} / "
          f"test {len(proto['test'])})")
    print("=" * 84)

    history, best = [], {"macro_f1": -1.0, "epoch": -1}
    epochs_done, patience = 0, 0
    stage2_best = -1.0
    run_t0 = time.perf_counter()

    for stage in (1, 2):
        if stage == 1:
            n_ep = CFG.stage1_epochs
            model.set_backbone_trainable(False)
            opt = torch.optim.AdamW(model.param_groups(lr_backbone, CFG.lr_head_stage1,
                                                       CFG.weight_decay), betas=(0.9, 0.999))
            sched = cosine_with_warmup(opt, n_ep * steps_per_epoch, 0)
        else:
            n_ep = CFG.stage2_epochs
            model.set_backbone_trainable(True)
            opt = torch.optim.AdamW(model.param_groups(lr_backbone, CFG.lr_head_stage2,
                                                       CFG.weight_decay), betas=(0.9, 0.999))
            sched = cosine_with_warmup(opt, n_ep * steps_per_epoch,
                                       int(CFG.warmup_frac * n_ep * steps_per_epoch))
            patience, stage2_best = 0, -1.0
        scaler = torch.amp.GradScaler("cuda") if USE_SCALER else None
        trainable = sum(p.numel() for p in model.parameters() if p.requires_grad)
        print(f"\n-- Stage {stage}: {n_ep} epochs, {trainable/1e6:.2f} M trainable parameters")

        for ep in range(n_ep):
            t_ep = time.perf_counter()
            tr_loss, tr_acc = train_one_epoch(model, train_loader, criterion, opt, sched, scaler)
            ev = evaluate(model, val_loader, criterion)
            vm = compute_metrics(ev["y_true"], ev["y_pred"], class_names=CLASSES)
            ep_time = time.perf_counter() - t_ep
            epochs_done += 1
            tracker.log_epoch(ep_time)
            history.append({"stage": stage, "epoch": epochs_done, "train_loss": tr_loss,
                            "train_acc": tr_acc, "val_loss": ev["loss"],
                            "val_acc": vm["accuracy"], "val_bacc": vm["balanced_accuracy"],
                            "val_macro_f1": vm["macro_f1"], "epoch_time_s": ep_time,
                            "lr": opt.param_groups[-1]["lr"]})
            improved = vm["macro_f1"] > best["macro_f1"] + CFG.early_stopping_min_delta
            flag = ""
            if improved:
                best = {"macro_f1": vm["macro_f1"], "epoch": epochs_done, "stage": stage,
                        "val_bacc": vm["balanced_accuracy"], "val_acc": vm["accuracy"]}
                torch.save({"model": model.state_dict(), "epoch": epochs_done, "stage": stage,
                            "val_macro_f1": vm["macro_f1"], "seed": seed, "key": key},
                           ckpt_dir / "best.pt")
                flag = "  <- best (checkpoint saved)"
            # Patience is measured against the best score achieved WITHIN stage 2.
            # Measuring it against the global best is a real failure mode: the frozen
            # stage-1 head often plateaus above the first few fine-tuning epochs (the
            # warm-up dip), which would trip early stopping after 3 epochs and ship a
            # linear probe labelled as a fine-tuned model - and it would bite the
            # low-LR backbones (DINOv3, Vision-RWKV) hardest, i.e. unfairly.
            if stage == 2:
                if vm["macro_f1"] > stage2_best + CFG.early_stopping_min_delta:
                    stage2_best, patience = vm["macro_f1"], 0
                else:
                    patience += 1
            print(f"   ep {epochs_done:2d}/{CFG.total_epochs} | train loss {tr_loss:.4f} "
                  f"acc {tr_acc:.4f} | val loss {ev['loss']:.4f} bAcc {vm['balanced_accuracy']:.4f} "
                  f"mF1 {vm['macro_f1']:.4f} | {ep_time:.1f}s{flag}")
            pd.DataFrame(history).to_csv(ckpt_dir / "history.csv", index=False)
            (ckpt_dir / "config.json").write_text(json.dumps({
                "run_id": run_id, "model_key": key, "display": info["display"],
                "weights": info["source"], "seed": seed, "gpu": GPU_NAME,
                "img_size": CFG.img_size, "batch_size": BATCH_SIZE,
                "epochs_planned": CFG.total_epochs, "epochs_done": epochs_done,
                "lr_backbone": lr_backbone, "lr_head_s1": CFG.lr_head_stage1,
                "lr_head_s2": CFG.lr_head_stage2, "weight_decay": CFG.weight_decay,
                "amp_dtype": str(AMP_DTYPE), "split_hash": proto["split_hash"],
                "protocol": proto["name"],
                "class_weights": proto["weights_np"].tolist(), "best": best,
            }, indent=2))
            if stage == 2 and patience >= CFG.early_stopping_patience:
                print(f"   early stopping: no val macro-F1 improvement for "
                      f"{CFG.early_stopping_patience} epochs")
                break
        if stage == 2 and patience >= CFG.early_stopping_patience:
            break

    run_time = time.perf_counter() - run_t0
    tracker.log_run(run_id, run_time)
    print(f"-- run finished in {fmt_hms(run_time)} | best val macro-F1 {best['macro_f1']:.4f} "
          f"@ epoch {best['epoch']}")
    print(f"-- estimated remaining training time: {tracker.eta_string()}")

    del model, backbone
    gc.collect(); torch.cuda.empty_cache()
    return {"run_id": run_id, "key": key, "seed": seed, "best": best,
            "protocol": proto["name"], "split_hash": proto["split_hash"],
            "epochs_done": epochs_done, "run_time_s": run_time,
            "mean_epoch_s": float(np.mean([h["epoch_time_s"] for h in history])),
            "history": history, "ckpt": str(ckpt_dir / "best.pt")}

### 9.2a Throughput calibration and measured compute projection

Before spending any real GPU time, this cell measures three numbers per architecture on
the actual runtime:

1. **dataloader-only throughput** — how fast the augmentation pipeline alone can feed batches;
2. **end-to-end training throughput** — the rate actually achieved by `train_one_epoch`;
3. **stage-1 (frozen backbone) throughput** — the forward-only rate.

It then projects the full benchmark's cost from those measurements. Two things matter here.
First, on Colab you pay for **wall-clock with a GPU attached**, not for GPU-busy seconds, so a
CPU-bound dataloader costs exactly as much as a saturated GPU. Second, if training is
dataloader-bound, then the `train_s_per_epoch` column of Table 7 measures this notebook's
input pipeline rather than the architectures — which would make an efficiency claim about
the models invalid. The cell flags that condition explicitly instead of letting it pass
silently into the results.

Cost of this cell: roughly 2-4 minutes, and it runs before any real training starts.

In [ ]:
# ============================================================================
# Cell 9.2a - Throughput calibration and projected compute budget (MEASURED)
# ============================================================================
CALIB_STEPS = 12          # timed steps per measurement, after warm-up
CALIB_WARMUP = 3

def _timed_loader_only(loader, steps, warmup):
    """Wall-clock cost of producing batches, with no model attached."""
    it, n = iter(loader), 0
    for _ in range(warmup):
        next(it, None)
    t0 = time.perf_counter()
    for _ in range(steps):
        b = next(it, None)
        if b is None:
            break
        n += b[1].size(0)
    return n / max(time.perf_counter() - t0, 1e-9)

def _timed_train_steps(model, loader, criterion, opt, scaler, steps, warmup, frozen):
    model.set_backbone_trainable(not frozen)
    model.train()
    if frozen:
        model.backbone.eval()
    it, n = iter(loader), 0
    for i in range(warmup + steps):
        batch = next(it, None)
        if batch is None:
            it = iter(loader); batch = next(it)
        if i == warmup:
            torch.cuda.synchronize(); t0 = time.perf_counter(); n = 0
        x, y, _ = batch
        x = x.to(DEVICE, non_blocking=True); y = y.to(DEVICE, non_blocking=True)
        opt.zero_grad(set_to_none=True)
        with torch.autocast("cuda", dtype=AMP_DTYPE, enabled=CFG.amp):
            loss = criterion(model(x).float(), y)
        if scaler is not None:
            scaler.scale(loss).backward(); scaler.step(opt); scaler.update()
        else:
            loss.backward(); opt.step()
        n += y.size(0)
    torch.cuda.synchronize()
    return n / max(time.perf_counter() - t0, 1e-9)

CALIB = {}
with Timer("throughput_calibration", TIMINGS, verbose=False):
    _, _eval_tf0 = build_transforms(IMAGENET_MEAN, IMAGENET_STD, CFG.img_size)
    _train_tf0, _ = build_transforms(IMAGENET_MEAN, IMAGENET_STD, CFG.img_size)
    _probe_loader = make_loader(train_df, _train_tf0, BATCH_SIZE, True, 0)
    loader_only = _timed_loader_only(_probe_loader, CALIB_STEPS, CALIB_WARMUP)
    del _probe_loader; gc.collect()
    print(f"Dataloader-only throughput ({CFG.num_workers} workers): {loader_only:7.1f} img/s")
    print(f"  -> pipeline floor for one training epoch: {len(train_df)/loader_only:6.1f} s\n")

    for key in AVAILABLE_MODELS:
        info = MODEL_INFO[key]
        set_all_seeds(CFG.lr_search_seed)
        tf_tr, _ = build_transforms(info["mean"], info["std"], CFG.img_size)
        loader = make_loader(train_df, tf_tr, BATCH_SIZE, True, 0)
        backbone, *_ = MODEL_BUILDERS[key](CFG.img_size)
        model = LesionClassifier(backbone, info["feat_dim"], NUM_CLASSES).to(DEVICE)
        crit = nn.CrossEntropyLoss(weight=CLASS_WEIGHTS)
        opt = torch.optim.AdamW(model.parameters(), lr=1e-5)
        scaler = torch.amp.GradScaler("cuda") if USE_SCALER else None
        thr_s2 = _timed_train_steps(model, loader, crit, opt, scaler,
                                    CALIB_STEPS, CALIB_WARMUP, frozen=False)
        opt = torch.optim.AdamW([p for p in model.head.parameters()], lr=1e-3)
        thr_s1 = _timed_train_steps(model, loader, crit, opt, scaler,
                                    CALIB_STEPS, CALIB_WARMUP, frozen=True)
        CALIB[key] = {"train_img_s": thr_s2, "frozen_img_s": thr_s1,
                      "bound": "dataloader" if thr_s2 > 0.85 * loader_only else "GPU"}
        print(f"  {info['display']:<26} stage-2 {thr_s2:7.1f} img/s | "
              f"stage-1 {thr_s1:7.1f} img/s | bound by {CALIB[key]['bound']}")
        del model, backbone, opt, loader; gc.collect(); torch.cuda.empty_cache()

# ---- project the full benchmark from these measurements ---------------------
def project_hours(seeds, s1_ep, s2_ep, models=None) -> float:
    models = models or AVAILABLE_MODELS
    total = 0.0
    for key in models:
        c = CALIB[key]
        val_s = len(val_df) / max(c["train_img_s"] * 2.0, 1.0)     # fwd-only, batch x2
        ep1 = len(train_df) / c["frozen_img_s"] + val_s
        ep2 = len(train_df) / c["train_img_s"] + val_s
        total += seeds * (s1_ep * ep1 + s2_ep * ep2)
    return total / 3600

train_h = project_hours(len(CFG.seeds), CFG.stage1_epochs, CFG.stage2_epochs)
lr_h = (project_hours(1, 1, CFG.lr_search_epochs) * len(CFG.lr_grid)) if CFG.lr_search else 0.0
infer_imgs = (len(test_df) + (len(ext_df) if EXT_AVAILABLE else 0)) * \
             len(AVAILABLE_MODELS) * len(CFG.seeds) * (1 + len(CORRUPTION_NAMES))
infer_thr = float(np.mean([c["train_img_s"] for c in CALIB.values()])) * 2.5
infer_h = infer_imgs / max(infer_thr, 1.0) / 3600

BUDGET = {"lr_search_h": lr_h, "training_h": train_h, "inference_h": infer_h,
          "total_h": lr_h + train_h + infer_h}
print("\n" + "=" * 78)
print("PROJECTED COMPUTE BUDGET (from measurements above, not from assumptions)")
print("=" * 78)
print(f"  LR search   ({len(CFG.lr_grid)} LRs x 1 seed x {CFG.lr_search_epochs} FT epochs) : "
      f"{lr_h:6.2f} GPU-h")
print(f"  Main training ({len(AVAILABLE_MODELS)} models x {len(CFG.seeds)} seeds x "
      f"{CFG.total_epochs} epochs)  : {train_h:6.2f} GPU-h")
print(f"  All inference ({infer_imgs:,} images)              : {infer_h:6.2f} GPU-h")
print(f"  {'TOTAL':<52} : {BUDGET['total_h']:6.2f} GPU-h")
print("  Early stopping can only reduce the training term.")
bound = [k for k, c in CALIB.items() if c["bound"] == "dataloader"]
if bound:
    print("\n  WARNING - dataloader-bound: " + ", ".join(MODEL_INFO[k]["display"] for k in bound))
    print("  For these models `train_s_per_epoch` in Table 7 measures THIS NOTEBOOK'S input")
    print("  pipeline, not the architecture. Raise CFG.num_workers, or report only")
    print("  latency/throughput (Section 14) as the architectural cost measures.")
if BUDGET["total_h"] > 20:
    print("\n  *** PROJECTION EXCEEDS THE 20 GPU-h CEILING - reduce seeds or epochs "
          "before running Section 9. ***")
save_table(pd.DataFrame([{"model": MODEL_INFO[k]["display"], **v} for k, v in CALIB.items()]),
           "table_throughput_calibration", "Measured throughput calibration")


Dataloader-only throughput (8 workers):   700.6 img/s
  -> pipeline floor for one training epoch:   10.0 s

    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  DINOv3 ViT-S/16            stage-2   478.9 img/s | stage-1   576.1 img/s | bound by GPU
  ConvNeXt V2-Tiny           stage-2   130.9 img/s | stage-1   518.1 img/s | bound by GPU
    [dinov3] token layout verified: 1 prefix (1 CLS + 0 register) + 196 patch tokens, width 384 -> feature dim 768
  DeiT III ViT-S/16          stage-2   509.2 img/s | stage-1   654.5 img/s | bound by GPU
  Swin-T                     stage-2   289.7 img/s | stage-1   551.0 img/s | bound by GPU
  ResNet-50                  stage-2   395.7 img/s | stage-1   583.4 img/s | bound by GPU
  EfficientNetV2-S           stage-2   300.6 img/s | stage-1   707.5 img/s | bound by GPU
  DenseNet-121               stage-2   344.5 img/s | stage-1   586.0 img/s | bound by GPU

PROJECTED COMPUTE BUDGET (from 

,model,train_img_s,frozen_img_s,bound
0,DINOv3 ViT-S/16,478.859677,576.056395,GPU
1,ConvNeXt V2-Tiny,130.894599,518.063816,GPU
2,DeiT III ViT-S/16,509.232249,654.549934,GPU
3,Swin-T,289.701439,550.987504,GPU
4,ResNet-50,395.708265,583.354523,GPU
5,EfficientNetV2-S,300.614480,707.506303,GPU
6,DenseNet-121,344.511542,586.021308,GPU


In [ ]:
# ============================================================================
# Cell 9.2a-2 - GATE B: measured compute budget
# ============================================================================
GPU_HOUR_CEILING = 20.0        # absolute ceiling
GPU_HOUR_TARGET = 10.0         # preferred

print("=" * 78)
print("GATE B - measured compute budget")
print("=" * 78)

_total = BUDGET["total_h"] + 0.6          # + Section 18 leakage ablation (4 models x 1 seed)
print(f"  Projected, including the Section 18 ablation: {_total:.2f} GPU-h")
gate("projection within the absolute ceiling", _total <= GPU_HOUR_CEILING,
     f"{_total:.2f} <= {GPU_HOUR_CEILING} GPU-h",
     "Reduce CFG.seeds or CFG.stage2_epochs, then re-run 9.2a.")
if _total > GPU_HOUR_TARGET:
    print(f"  [WARN] above the {GPU_HOUR_TARGET} GPU-h preferred target - acceptable, but check "
          "that the extra spend buys something.")

_bound = [k for k, c in CALIB.items() if c["bound"] == "dataloader"]
if _bound:
    print(f"  [WARN] dataloader-bound: "
          f"{', '.join(MODEL_INFO[k]['display'] for k in _bound)}")
    print(f"         CFG.num_workers = {CFG.num_workers}, os.cpu_count() = {os.cpu_count()}")
    print("         Consequence: `train_s_per_epoch` in Table 7 measures THIS notebook's input")
    print("         pipeline, not the architecture. Either raise CFG.num_workers and re-run 9.2a,")
    print("         or report only latency and throughput as the architectural cost measures.")
    print("         This does not affect accuracy results - only the efficiency claim.")
else:
    gate("no model is dataloader-bound", True, "epoch times are architecture-limited")

gate("throughput measured for every available model",
     all(k in CALIB for k in AVAILABLE_MODELS),
     f"{len(CALIB)}/{len(AVAILABLE_MODELS)} measured")

print("\nGate B passed. Proceed to Stage 5b (the smoke test in 9.2b).")


GATE B - measured compute budget
  Projected, including the Section 18 ablation: 6.64 GPU-h
  [PASS] projection within the absolute ceiling  -- 6.64 <= 20.0 GPU-h
  [PASS] no model is dataloader-bound  -- epoch times are architecture-limited
  [PASS] throughput measured for every available model  -- 7/7 measured

Gate B passed. Proceed to Stage 5b (the smoke test in 9.2b).


### 9.2b Pipeline smoke test

`run_experiment` was parameterised by evaluation protocol so that Section 18's ablation runs
through the identical code path. That parameterisation has never been executed. Every other risky
component — the model builders, the corruption cache, the statistics — is either already exercised
by an earlier cell or cheap to redo, but a bug in the training loop would only surface hours into
Stage 6.

This cell therefore runs one model for two epochs through **both** protocol paths, then deletes
what it created. Roughly 3–5 minutes, and it is the cheapest insurance in the notebook.

It also temporarily fills `BACKBONE_LR` with a placeholder, because the real values are not
selected until 9.2c. Those placeholders are discarded at the end of the cell.

In [ ]:
RUN_SMOKE_TEST = True

if RUN_SMOKE_TEST and AVAILABLE_MODELS:
    _saved = (CFG.stage1_epochs, CFG.stage2_epochs, CFG.total_epochs,
              dict(globals().get("BACKBONE_LR", {})))
    _key = ("convnextv2_tiny" if "convnextv2_tiny" in AVAILABLE_MODELS
            else AVAILABLE_MODELS[0])          # the lowest-risk backbone available
    _seed = CFG.seeds[0]
    _ids = []
    try:
        CFG.stage1_epochs, CFG.stage2_epochs = 1, 1
        BACKBONE_LR = {k: 3e-5 for k in AVAILABLE_MODELS}   # placeholder; 9.2c overwrites it
        _tracker = RunTracker(2, 2)

        print("=" * 78)
        print(f"SMOKE TEST 1/2 - default (lesion-disjoint) protocol, {MODEL_INFO[_key]['display']}")
        print("=" * 78)
        _r1 = run_experiment(_key, _seed, _tracker)
        _ids.append(_r1["run_id"])

        print("\n" + "=" * 78)
        print("SMOKE TEST 2/2 - an alternative protocol, exercising the Section 18 code path")
        print("=" * 78)
        _proto = make_protocol(train_df.head(400), val_df.head(120), test_df,
                               "SMOKETEST0000000", "smoke-test protocol", "_smoke")
        _r2 = run_experiment(_key, _seed, _tracker, protocol=_proto)
        _ids.append(_r2["run_id"])

        print("\n" + "=" * 78)
        print("SMOKE TEST RESULT")
        print("=" * 78)
        gate("default protocol completes", _r1["epochs_done"] == 2,
             f"{_r1['epochs_done']} epochs, best val macro-F1 {_r1['best']['macro_f1']:.4f}")
        gate("alternative protocol completes", _r2["epochs_done"] == 2,
             f"{_r2['epochs_done']} epochs, best val macro-F1 {_r2['best']['macro_f1']:.4f}")
        gate("the two runs used different protocols",
             _r1["split_hash"] != _r2["split_hash"],
             f"{_r1['split_hash']} vs {_r2['split_hash']}",
             "Both runs used the same split - the protocol argument is not taking effect, "
             "so Section 18 would compare a split against itself.")
        gate("checkpoints written for both runs",
             all((CFG.ckpt_dir / rid / "best.pt").exists() for rid in _ids),
             ", ".join(_ids))
        _cfg2 = json.loads((CFG.ckpt_dir / _r2["run_id"] / "config.json").read_text())
        gate("config.json records the protocol",
             _cfg2.get("protocol") == "smoke-test protocol",
             f"recorded: {_cfg2.get('protocol')!r}")
    finally:
        (CFG.stage1_epochs, CFG.stage2_epochs, _, _restore) = _saved
        BACKBONE_LR = _restore                       # discard the placeholder LRs
        for rid in _ids:                             # remove smoke-test checkpoints, or the
            shutil.rmtree(CFG.ckpt_dir / rid, ignore_errors=True)   # provenance guard in 9.3
        print(f"\nCleaned up {len(_ids)} smoke-test checkpoint director"
              f"{'y' if len(_ids) == 1 else 'ies'}; "
              f"epoch budget restored to {CFG.stage1_epochs}+{CFG.stage2_epochs}.")
        gc.collect()
        if torch.cuda.is_available():
            torch.cuda.empty_cache()
    print("\nSmoke test passed. Proceed to Stage 5c (the LR search in 9.2c).")
else:
    print("Smoke test skipped (RUN_SMOKE_TEST = False or no models available).")
    print("The protocol parameterisation used by Section 18 is then unverified until 9.3 runs.")

SMOKE TEST 1/2 - default (lesion-disjoint) protocol, ConvNeXt V2-Tiny

EXPERIMENT
  Model        : ConvNeXt V2-Tiny   [Modern CNN]
  Weights      : timm:convnextv2_tiny.fcmae_ft_in22k_in1k
  Seed         : 42
  GPU          : NVIDIA L4
  Image size   : 224
  Epochs       : 2 (1 frozen + 1 FT)
  Batch size   : 64
  LR           : head 0.001/0.0001 | backbone 3e-05
  Protocol     : lesion-disjoint
  Split        : 15d11636eef01b57  (train 7009 / val 1498 / test 1508)

-- Stage 1: 1 epochs, 0.01 M trainable parameters


train:   0%|          | 0/110 [00:00<?, ?it/s]

   ep  1/2 | train loss 1.5206 acc 0.5379 | val loss 1.2706 bAcc 0.5745 mF1 0.4277 | 51.8s  <- best (checkpoint saved)

-- Stage 2: 1 epochs, 27.87 M trainable parameters


train:   0%|          | 0/110 [00:00<?, ?it/s]

   ep  2/2 | train loss 1.0157 acc 0.6788 | val loss 0.8559 bAcc 0.6936 mF1 0.5512 | 86.6s  <- best (checkpoint saved)
-- run finished in 0h 02m 19s | best val macro-F1 0.5512 @ epoch 2
-- estimated remaining training time: 0h 02m 18s (upper bound: 2 epochs x 69.2s mean; early stopping can only reduce this)

SMOKE TEST 2/2 - an alternative protocol, exercising the Section 18 code path

EXPERIMENT
  Model        : ConvNeXt V2-Tiny   [Modern CNN]
  Weights      : timm:convnextv2_tiny.fcmae_ft_in22k_in1k
  Seed         : 42
  GPU          : NVIDIA L4
  Image size   : 224
  Epochs       : 2 (1 frozen + 1 FT)
  Batch size   : 64
  LR           : head 0.001/0.0001 | backbone 3e-05
  Protocol     : smoke-test protocol
  Split        : SMOKETEST0000000  (train 400 / val 120 / test 1508)

-- Stage 1: 1 epochs, 0.01 M trainable parameters


train:   0%|          | 0/7 [00:00<?, ?it/s]

   ep  1/2 | train loss 1.0771 acc 0.8775 | val loss 0.3451 bAcc 1.0000 mF1 0.1429 | 21.1s  <- best (checkpoint saved)

-- Stage 2: 1 epochs, 27.87 M trainable parameters


train:   0%|          | 0/7 [00:00<?, ?it/s]

   ep  2/2 | train loss 0.6027 acc 0.9975 | val loss 0.0599 bAcc 1.0000 mF1 0.1429 | 26.5s
-- run finished in 0h 00m 48s | best val macro-F1 0.1429 @ epoch 1
-- estimated remaining training time: 0h 00m 00s (upper bound: 0 epochs x 46.5s mean; early stopping can only reduce this)

SMOKE TEST RESULT
  [PASS] default protocol completes  -- 2 epochs, best val macro-F1 0.5512
  [PASS] alternative protocol completes  -- 2 epochs, best val macro-F1 0.1429
  [PASS] the two runs used different protocols  -- 15d11636eef01b57 vs SMOKETEST0000000
  [PASS] checkpoints written for both runs  -- convnextv2_tiny_seed42, convnextv2_tiny_seed42_smoke
  [PASS] config.json records the protocol  -- recorded: 'smoke-test protocol'

Cleaned up 2 smoke-test checkpoint directories; epoch budget restored to 4+16.

Smoke test passed. Proceed to Stage 5c (the LR search in 9.2c).


### 9.2c Backbone learning rate, selected on validation with an equal budget

The previous version hard-coded two learning rates by architecture *family*
(`1e-5` for DINOv3 and Vision-RWKV, `5e-5` for ConvNeXt V2 and MambaVision). That is a
fairness defect in a benchmark whose headline claim is a comparison *between* those
architectures: any difference in the results confounds the architecture with the learning
rate it happened to be assigned, and the stated justification — preserving self-supervised
features — does not even apply to Vision-RWKV, which is supervised ImageNet-1k pretrained.

Each architecture therefore receives the **same** search budget over the **same** grid, and
the winner is chosen on **validation** macro-F1. The test set is not touched; `GUARD` still
blocks it. One seed is used, since this is a screening step, not a reported result.

The selected LR per model is recorded in the manifest, so the choice is auditable.
Set `CFG.lr_search = False` to skip the search and use `CFG.lr_backbone_default`
uniformly — also fair, just less favourable to every model.

In [ ]:
# ============================================================================
# Cell 9.2c - Select the backbone LR per model on VALIDATION (never on test)
# ============================================================================
def probe_lr(key: str, lr: float, seed: int, n_ft_epochs: int) -> float:
    """Short stage-1 + stage-2 probe; returns the best VALIDATION macro-F1."""
    info = MODEL_INFO[key]
    set_all_seeds(seed)
    tf_tr, tf_ev = build_transforms(info["mean"], info["std"], CFG.img_size)
    tl = make_loader(train_df, tf_tr, BATCH_SIZE, True, seed)
    vl = make_loader(val_df, tf_ev, BATCH_SIZE * 2, False, seed)
    backbone, *_ = MODEL_BUILDERS[key](CFG.img_size)
    model = LesionClassifier(backbone, info["feat_dim"], NUM_CLASSES).to(DEVICE)
    crit = nn.CrossEntropyLoss(weight=CLASS_WEIGHTS, label_smoothing=CFG.label_smoothing)
    best = -1.0
    # one frozen epoch so the head is not random when the backbone unfreezes
    model.set_backbone_trainable(False)
    opt = torch.optim.AdamW(model.param_groups(lr, CFG.lr_head_stage1, CFG.weight_decay))
    sc = cosine_with_warmup(opt, STEPS_PER_EPOCH, 0)
    scaler = torch.amp.GradScaler("cuda") if USE_SCALER else None
    train_one_epoch(model, tl, crit, opt, sc, scaler)
    # short fine-tuning at the candidate backbone LR
    model.set_backbone_trainable(True)
    opt = torch.optim.AdamW(model.param_groups(lr, CFG.lr_head_stage2, CFG.weight_decay))
    total = n_ft_epochs * STEPS_PER_EPOCH
    sc = cosine_with_warmup(opt, total, int(CFG.warmup_frac * total))
    scaler = torch.amp.GradScaler("cuda") if USE_SCALER else None
    for _ in range(n_ft_epochs):
        train_one_epoch(model, tl, crit, opt, sc, scaler)
        ev = evaluate(model, vl, crit)
        best = max(best, compute_metrics(ev["y_true"], ev["y_pred"], class_names=CLASSES)["macro_f1"])
    del model, backbone, opt, tl, vl
    gc.collect(); torch.cuda.empty_cache()
    return best

BACKBONE_LR: dict[str, float] = {}
lr_rows = []
if CFG.lr_search:
    print("=" * 84)
    print(f"BACKBONE LR SEARCH - grid {list(CFG.lr_grid)}, seed {CFG.lr_search_seed}, "
          f"{CFG.lr_search_epochs} fine-tuning epochs per point")
    print("  Selection criterion: VALIDATION macro-F1. The test set is not read.")
    print("=" * 84)
    with Timer("lr_search", TIMINGS, verbose=False):
        for key in AVAILABLE_MODELS:
            scores = {}
            for lr in CFG.lr_grid:
                t0 = time.perf_counter()
                scores[lr] = probe_lr(key, lr, CFG.lr_search_seed, CFG.lr_search_epochs)
                print(f"  {MODEL_INFO[key]['display']:<26} lr={lr:.0e} -> "
                      f"val macro-F1 {scores[lr]:.4f}   ({fmt_hms(time.perf_counter()-t0)})")
                lr_rows.append({"model": MODEL_INFO[key]["display"], "lr": lr,
                                "val_macro_f1": scores[lr]})
            BACKBONE_LR[key] = max(scores, key=scores.get)
            _edge = BACKBONE_LR[key] in (min(CFG.lr_grid), max(CFG.lr_grid))
            print(f"  -> selected {BACKBONE_LR[key]:.0e} for {MODEL_INFO[key]['display']}"
                  + ("  <- AT THE GRID BOUNDARY" if _edge else ""))
            if _edge:
                print("     A search that ends on its own edge has not located an optimum.")
                print("     Widen CFG.lr_grid in that direction and re-run this cell, or")
                print("     report the result as 'best within the searched range'.")
            print()
else:
    BACKBONE_LR = {k: CFG.lr_backbone_default for k in AVAILABLE_MODELS}
    print(f"LR search disabled - every backbone uses {CFG.lr_backbone_default:g} "
          f"(uniform, therefore still fair).")

if lr_rows:
    lr_tab = pd.DataFrame(lr_rows)
    chosen = {MODEL_INFO[k]["display"]: v for k, v in BACKBONE_LR.items()}
    lr_tab["selected"] = [chosen[m] == lr for m, lr in zip(lr_tab.model, lr_tab.lr)]
else:
    lr_tab = pd.DataFrame([{"model": MODEL_INFO[k]["display"], "lr": v,
                            "val_macro_f1": np.nan, "selected": True}
                           for k, v in BACKBONE_LR.items()])
save_table(lr_tab, "table2b_lr_selection",
           "Backbone LR selection on validation (equal budget per architecture)")
print("Selected backbone learning rates:",
      {MODEL_INFO[k]["display"]: f"{v:.0e}" for k, v in BACKBONE_LR.items()})


BACKBONE LR SEARCH - grid [3e-05, 0.0001, 0.0003, 0.001], seed 42, 3 fine-tuning epochs per point
  Selection criterion: VALIDATION macro-F1. The test set is not read.


train:   0%|          | 0/110 [00:00<?, ?it/s]

    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768


train:   0%|          | 0/110 [00:00<?, ?it/s]

train:   0%|          | 0/110 [00:00<?, ?it/s]

...

train:   0%|          | 0/110 [00:00<?, ?it/s]

train:   0%|          | 0/110 [00:00<?, ?it/s]

train:   0%|          | 0/110 [00:00<?, ?it/s]

train:   0%|          | 0/110 [00:00<?, ?it/s]

  DenseNet-121               lr=1e-03 -> val macro-F1 0.6194   (0h 02m 32s)
  -> selected 3e-04 for DenseNet-121

Selected backbone learning rates: {'DINOv3 ViT-S/16': '1e-04', 'ConvNeXt V2-Tiny': '1e-04', 'DeiT III ViT-S/16': '1e-04', 'Swin-T': '1e-04', 'ResNet-50': '1e-03', 'EfficientNetV2-S': '3e-04', 'DenseNet-121': '3e-04'}


### 9.2 Main training loop

`len(AVAILABLE_MODELS) x len(CFG.seeds)` runs of up to 20 epochs each (4 frozen + up to 16 fine-tuning, early stopping on validation macro-F1). Progress, per-epoch timing, and a
measured ETA are printed continuously. If the runtime disconnects, re-running this cell resumes
from the runs that still have no `best.pt`.

In [ ]:
# ============================================================================
# Cell 9.3 - Train every (model, seed) combination
# ============================================================================
RESULTS: dict[str, dict] = {}
tracker = RunTracker(len(AVAILABLE_MODELS) * len(CFG.seeds), CFG.total_epochs)

print(f"Planned: {len(AVAILABLE_MODELS)} models x {len(CFG.seeds)} seeds "
      f"= {len(AVAILABLE_MODELS) * len(CFG.seeds)} runs, "
      f"<= {tracker.planned_epochs} epochs total\n")

with Timer("training_total", TIMINGS, verbose=False):
    for key in AVAILABLE_MODELS:
        for seed in CFG.seeds:
            run_id = f"{key}_seed{seed}"
            done = CFG.ckpt_dir / run_id / "history.csv"
            cfg_path = CFG.ckpt_dir / run_id / "config.json"
            reusable, why = False, ""
            if (CFG.ckpt_dir / run_id / "best.pt").exists() and done.exists():
                # A stale checkpoint from a different split or a different backbone LR would
                # silently corrupt the benchmark, so provenance is checked before reuse.
                try:
                    prev = json.loads(cfg_path.read_text())
                    same_split = prev.get("split_hash") == SPLIT_HASH
                    same_lr = abs(float(prev.get("lr_backbone", -1))
                                  - BACKBONE_LR[key]) < 1e-12
                    same_bs = int(prev.get("batch_size", -1)) == BATCH_SIZE
                    reusable = same_split and same_lr and same_bs
                    if not reusable:
                        why = (f"split_hash {'ok' if same_split else 'MISMATCH'}, "
                               f"lr_backbone {'ok' if same_lr else 'MISMATCH'}, "
                               f"batch_size {'ok' if same_bs else 'MISMATCH'}")
                except Exception as e:  # noqa: BLE001
                    why = f"unreadable config.json ({type(e).__name__})"
            if not reusable and why:
                print(f"[retrain] {run_id}: existing checkpoint rejected - {why}")
            if reusable:
                hist = pd.read_csv(done)
                print(f"[skip] {run_id} already trained ({len(hist)} epochs on disk, "
                      f"split {SPLIT_HASH}, lr {BACKBONE_LR[key]:.0e})")
                RESULTS[run_id] = {"run_id": run_id, "key": key, "seed": seed,
                                   "best": {"macro_f1": float(hist.val_macro_f1.max()),
                                            "epoch": int(hist.val_macro_f1.idxmax()) + 1},
                                   "epochs_done": len(hist),
                                   "run_time_s": float(hist.epoch_time_s.sum()),
                                   "mean_epoch_s": float(hist.epoch_time_s.mean()),
                                   "history": hist.to_dict("records"),
                                   "ckpt": str(CFG.ckpt_dir / run_id / "best.pt")}
                continue
            RESULTS[run_id] = run_experiment(key, seed, tracker)

GUARD.training_complete = True   # the test set is unlocked only from here on
print("\n" + "=" * 84)
print(f"TRAINING COMPLETE - {len(RESULTS)} runs, {len(tracker.epoch_times)} epochs measured")
print(f"Wall-clock training time : {fmt_hms(TIMINGS.get('training_total', 0.0))}")
print(f"Mean epoch time          : {tracker.mean_epoch:.1f} s")
print("Test-set access is now authorised for evaluation only.")
print("=" * 84)
json.dump({k: {kk: vv for kk, vv in v.items() if kk != "history"} for k, v in RESULTS.items()},
          open(CFG.out_dir / "run_summary.json", "w"), indent=2, default=str)

Planned: 7 models x 5 seeds = 35 runs, <= 700 epochs total


EXPERIMENT
  Model        : DINOv3 ViT-S/16   [Self-supervised ViT (foundation model)]
  Weights      : timm:vit_small_patch16_dinov3.lvd1689m
  Seed         : 42
  GPU          : NVIDIA L4
  Image size   : 224
  Epochs       : 20 (4 frozen + 16 FT)
  Batch size   : 64
  LR           : head 0.001/0.0001 | backbone 0.0001
  Protocol     : lesion-disjoint
  Split        : 15d11636eef01b57  (train 7009 / val 1498 / test 1508)

-- Stage 1: 4 epochs, 0.01 M trainable parameters


train:   0%|          | 0/110 [00:00<?, ?it/s]

    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
   ep  1/20 | train loss 1.3636 acc 0.5641 | val loss 1.2014 bAcc 0.5796 mF1 0.3789 | 22.0s  <- best (checkpoint saved)


train:   0%|          | 0/110 [00:00<?, ?it/s]

   ep  2/20 | train loss 0.9696 acc 0.6750 | val loss 1.0841 bAcc 0.5977 mF1 0.4957 | 21.0s  <- best (checkpoint saved)


...

   ep 17/20 | train loss 0.0882 acc 0.9456 | val loss 0.7904 bAcc 0.6820 mF1 0.6994 | 29.9s


train:   0%|          | 0/110 [00:00<?, ?it/s]

   ep 18/20 | train loss 0.0691 acc 0.9513 | val loss 0.7700 bAcc 0.6848 mF1 0.7045 | 30.2s


train:   0%|          | 0/110 [00:00<?, ?it/s]

   ep 19/20 | train loss 0.0619 acc 0.9585 | val loss 0.7464 bAcc 0.6790 mF1 0.7073 | 30.2s
   early stopping: no val macro-F1 improvement for 3 epochs
-- run finished in 0h 08m 58s | best val macro-F1 0.7174 @ epoch 16
-- estimated remaining training time: 1h 00m 48s (upper bound: 121 epochs x 30.1s mean; early stopping can only reduce this)

TRAINING COMPLETE - 35 runs, 579 epochs measured
Wall-clock training time : 4h 52m 37s
Mean epoch time          : 30.1 s
Test-set access is now authorised for evaluation only.


In [ ]:
# ============================================================================
# Cell 9.4 - Training curves (per model, all seeds)
# ============================================================================
if RESULTS:
    n = len(AVAILABLE_MODELS)
    fig, axes = plt.subplots(2, n, figsize=(5.0 * n, 8), squeeze=False)
    for j, key in enumerate(AVAILABLE_MODELS):
        for seed in CFG.seeds:
            r = RESULTS.get(f"{key}_seed{seed}")
            if not r:
                continue
            h = pd.DataFrame(r["history"])
            axes[0][j].plot(h.epoch, h.train_loss, "--", alpha=0.65, label=f"train s{seed}")
            axes[0][j].plot(h.epoch, h.val_loss, "-", label=f"val s{seed}")
            axes[1][j].plot(h.epoch, h.val_macro_f1, "-o", ms=3, label=f"seed {seed}")
        axes[0][j].axvline(CFG.stage1_epochs + 0.5, color="grey", ls=":", lw=1)
        axes[1][j].axvline(CFG.stage1_epochs + 0.5, color="grey", ls=":", lw=1)
        axes[0][j].set_title(MODEL_INFO[key]["display"]); axes[0][j].set_ylabel("loss")
        axes[1][j].set_ylabel("validation macro-F1"); axes[1][j].set_xlabel("epoch")
        for a in (axes[0][j], axes[1][j]):
            a.grid(alpha=0.3); a.legend(fontsize=7)
    axes[0][0].text(0.02, 0.02, "dotted line = stage 1 -> stage 2", transform=axes[0][0].transAxes,
                    fontsize=8, color="grey")
    plt.tight_layout()
    plt.savefig(CFG.fig_dir / "figure_training_curves.png", dpi=300, bbox_inches="tight")
    plt.show()

---
## 10. HAM10000 Evaluation

### 10.1 Protocol

For each of the `models x 5 seeds` runs, the checkpoint with the best **validation** macro-F1 is
restored and applied once to the held-out test partition. Per-image probabilities are written to
`results/predictions/` because Section 12 (McNemar) and Section 13 (robustness) need the paired,
per-example predictions rather than aggregate scores.

### 10.2 How the confidence intervals are computed

For each metric we have `n = 5` observations, one per seed. We report:

* **mean** across seeds,
* **SD** — the *sample* standard deviation (`ddof = 1`),
* **95 % CI** — a Student-*t* interval on the mean of the seeds:

> `CI = mean ± t(0.975, df = n − 1) · SD / √n`, with `t(0.975, 4) = 2.776`.

This interval quantifies **training-run variability only** — the uncertainty introduced by random
initialisation of the head, data ordering, and augmentation sampling. It does **not** capture
sampling uncertainty of the test set itself (the test set is identical across seeds by design).
With `n = 5` the interval is still wide and the *t* multiplier is still large; this is reported honestly rather
than replaced with a narrower but unjustified normal-approximation interval. Where test-set
sampling uncertainty matters, the McNemar test in Section 12 is the appropriate instrument, since
it operates on paired per-example outcomes.

In [ ]:
# ============================================================================
# Cell 10.1 - Test-set inference for every run
# ============================================================================
from scipy import stats as sstats

def load_run_model(key: str, seed: int):
    info = MODEL_INFO[key]
    backbone, *_ = MODEL_BUILDERS[key](CFG.img_size)
    model = LesionClassifier(backbone, info["feat_dim"], NUM_CLASSES).to(DEVICE)
    ckpt = torch.load(CFG.ckpt_dir / f"{key}_seed{seed}" / "best.pt", map_location=DEVICE,
                      weights_only=False)
    model.load_state_dict(ckpt["model"])
    model.eval()
    return model, ckpt

TEST_PRED: dict[str, dict] = {}
with Timer("evaluation_ham_test", TIMINGS, verbose=False):
    for key in AVAILABLE_MODELS:
        info = MODEL_INFO[key]
        _, eval_tf = build_transforms(info["mean"], info["std"], CFG.img_size)
        GUARD.authorise(f"HAM10000 test inference [{key}]")
        test_loader = make_loader(test_df, eval_tf, BATCH_SIZE * 2, False, 0)
        for seed in CFG.seeds:
            rid = f"{key}_seed{seed}"
            if not (CFG.ckpt_dir / rid / "best.pt").exists():
                continue
            model, _ = load_run_model(key, seed)
            ev = evaluate(model, test_loader, return_probs=True)
            TEST_PRED[rid] = {"key": key, "seed": seed, "y_true": ev["y_true"],
                              "y_pred": ev["y_pred"], "probs": ev["probs"],
                              "image_id": test_df.image_id.values}
            np.savez_compressed(CFG.pred_dir / f"{rid}_ham_test.npz",
                                y_true=ev["y_true"], y_pred=ev["y_pred"], probs=ev["probs"],
                                image_id=test_df.image_id.values)
            acc = (ev["y_pred"] == ev["y_true"]).mean()
            print(f"  {rid:<28} test accuracy {acc:.4f}")
            del model; gc.collect(); torch.cuda.empty_cache()
print(f"\nTest predictions stored for {len(TEST_PRED)} runs -> {CFG.pred_dir}")
print("GUARD:", GUARD.report())

    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed42         test accuracy 0.7593
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed123        test accuracy 0.8210
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed2024       test accuracy 0.8355
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed7          test accuracy 0.7938
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed2718       test accuracy 0.8369
  convnextv2_tiny_seed42       test accuracy 0.8229
  convnextv2_tiny_seed123      test accuracy 0.7633
  convnextv2_tiny_seed2024     test accuracy 0.8150
  convnex

In [ ]:
# ============================================================================
# Cell 10.2 - Table 3: HAM10000 test performance (mean +/- SD [95% CI])
# ============================================================================
def mean_sd_ci(values, level: float = 0.95):
    v = np.asarray([x for x in values if x is not None and np.isfinite(x)], dtype=float)
    n = len(v)
    if n == 0:
        return np.nan, np.nan, (np.nan, np.nan), 0
    mean = float(v.mean())
    if n == 1:
        return mean, np.nan, (np.nan, np.nan), 1
    sd = float(v.std(ddof=1))
    tcrit = float(sstats.t.ppf(0.5 + level / 2, df=n - 1))
    half = tcrit * sd / math.sqrt(n)
    return mean, sd, (mean - half, mean + half), n

PER_RUN_METRICS = {rid: compute_metrics(d["y_true"], d["y_pred"], d["probs"], class_names=CLASSES)
                   for rid, d in TEST_PRED.items()}
per_run_df = pd.DataFrame([{"run_id": rid, "model": MODEL_INFO[d["key"]]["display"],
                            "key": d["key"], "seed": d["seed"],
                            **{k: v for k, v in PER_RUN_METRICS[rid].items()
                               if not isinstance(v, (list, str))}}
                           for rid, d in TEST_PRED.items()])
save_table(per_run_df, "table3b_per_seed_results", "Per-seed HAM10000 test results (all runs shown)")

HEADLINE = ["accuracy", "balanced_accuracy", "macro_precision", "macro_recall",
            "macro_f1", "weighted_f1", "roc_auc_macro_ovr"]
rows = []
for key in AVAILABLE_MODELS:
    row = {"model": MODEL_INFO[key]["display"], "family": MODEL_INFO[key]["family"],
           "seeds": len([r for r in TEST_PRED.values() if r["key"] == key])}
    for m in HEADLINE:
        vals = [PER_RUN_METRICS[rid].get(m, np.nan) for rid, d in TEST_PRED.items() if d["key"] == key]
        mean, sd, ci, n = mean_sd_ci(vals, CFG.ci_level)
        row[m] = mean
        row[f"{m}_sd"] = sd
        row[f"{m}_ci_lo"], row[f"{m}_ci_hi"] = ci
        row[f"{m}_str"] = ("n/a" if not np.isfinite(mean) else
                           f"{mean:.4f} +/- {sd:.4f} [{ci[0]:.4f}, {ci[1]:.4f}]"
                           if np.isfinite(sd) else f"{mean:.4f}")
    rows.append(row)
for key, err in EXCLUDED_MODELS.items():
    rows.append({"model": f"{key} (EXCLUDED)", "family": MODEL_FAMILY[key], "seeds": 0,
                 **{f"{m}_str": "EXCLUDED" for m in HEADLINE}})
tab3_full = pd.DataFrame(rows)
tab3 = tab3_full[["model", "family", "seeds"] + [f"{m}_str" for m in HEADLINE]]
tab3.columns = ["Model", "Family", "Seeds", "Accuracy", "Balanced Acc.", "Macro Prec.",
                "Macro Rec.", "Macro F1", "Weighted F1", "ROC-AUC (macro OvR)"]

print("=" * 150)
print(f"TABLE 3 - HAM10000 test performance | mean +/- SD [{CFG.ci_level:.0%} CI] over "
      f"{len(CFG.seeds)} seeds (n={len(test_df)} images)")
print("=" * 150)
print(tab3.to_string(index=False))
print("=" * 150)
save_table(tab3, "table3_ham10000_test_performance",
           f"Table 3 - HAM10000 test performance, mean +/- SD [{CFG.ci_level:.0%} CI], "
           f"{len(CFG.seeds)} seeds")
save_table(tab3_full, "table3_ham10000_test_performance_full")

print("\nPer-class F1 / sensitivity / specificity (mean over seeds):")
pc_rows = []
for key in AVAILABLE_MODELS:
    rids = [rid for rid, d in TEST_PRED.items() if d["key"] == key]
    for c in CLASSES:
        pc_rows.append({
            "model": MODEL_INFO[key]["display"], "class": c,
            "support_test": int((test_df.label == c).sum()),
            "f1": np.mean([PER_RUN_METRICS[r][f"f1_{c}"] for r in rids]),
            "sensitivity": np.mean([PER_RUN_METRICS[r][f"sensitivity_{c}"] for r in rids]),
            "specificity": np.mean([PER_RUN_METRICS[r][f"specificity_{c}"] for r in rids]),
        })
pc_df = pd.DataFrame(pc_rows)
print(pc_df.pivot(index="class", columns="model", values="f1").round(4).to_string())
save_table(pc_df, "table3c_per_class_metrics", "Per-class F1 / sensitivity / specificity")

In [ ]:
# ============================================================================
# Cell 10.3 - Figure 1: confusion matrices (raw + row-normalised)
# ============================================================================
def plot_cm(ax, cm, title, normalize=False, cmap="Blues"):
    m = cm.astype(float)
    if normalize:
        m = m / np.clip(m.sum(1, keepdims=True), 1, None)
    im = ax.imshow(m, cmap=cmap, vmin=0, vmax=1 if normalize else None)
    ax.set_xticks(range(NUM_CLASSES)); ax.set_yticks(range(NUM_CLASSES))
    ax.set_xticklabels(CLASSES, rotation=45, ha="right", fontsize=8)
    ax.set_yticklabels(CLASSES, fontsize=8)
    thr = m.max() / 2 if m.max() > 0 else 0.5
    for i in range(NUM_CLASSES):
        for j in range(NUM_CLASSES):
            ax.text(j, i, f"{m[i, j]:.2f}" if normalize else f"{int(round(m[i, j]))}",
                    ha="center", va="center", fontsize=7,
                    color="white" if m[i, j] > thr else "black")
    ax.set_title(title, fontsize=9)
    ax.set_xlabel("predicted"); ax.set_ylabel("true")
    return im

if AVAILABLE_MODELS:
    n = len(AVAILABLE_MODELS)
    fig, axes = plt.subplots(2, n, figsize=(4.4 * n, 9), squeeze=False)
    CM_SUM = {}
    for j, key in enumerate(AVAILABLE_MODELS):
        rids = [rid for rid, d in TEST_PRED.items() if d["key"] == key]
        cm = np.sum([np.array(PER_RUN_METRICS[r]["confusion_matrix"]) for r in rids], axis=0)
        cm = cm / len(rids)
        CM_SUM[key] = cm
        plot_cm(axes[0][j], cm, f"{MODEL_INFO[key]['display']}\ncounts (mean over seeds)")
        plot_cm(axes[1][j], cm, f"{MODEL_INFO[key]['display']}\nrow-normalised (= sensitivity)",
                normalize=True, cmap="viridis")
    plt.suptitle("Figure 1 - HAM10000 test confusion matrices", fontsize=13, y=1.005)
    plt.tight_layout()
    plt.savefig(CFG.fig_dir / "figure1_confusion_matrices.png", dpi=300, bbox_inches="tight")
    plt.show()

In [ ]:
# ============================================================================
# Cell 10.4 - Figure 2: one-vs-rest ROC curves
# ============================================================================
if AVAILABLE_MODELS:
    fig, axes = plt.subplots(2, 4, figsize=(19, 9))
    axes = axes.ravel()
    colors = plt.cm.tab10(np.linspace(0, 1, max(len(AVAILABLE_MODELS), 3)))
    for i, c in enumerate(CLASSES):
        ax = axes[i]
        for m_i, key in enumerate(AVAILABLE_MODELS):
            rids = [rid for rid, d in TEST_PRED.items() if d["key"] == key]
            probs = np.mean([TEST_PRED[r]["probs"] for r in rids], axis=0)
            y = (TEST_PRED[rids[0]]["y_true"] == i).astype(int)
            if y.sum() == 0 or y.sum() == len(y):
                continue
            fpr, tpr, _ = roc_curve(y, probs[:, i])
            auc = roc_auc_score(y, probs[:, i])
            ax.plot(fpr, tpr, color=colors[m_i], lw=1.6,
                    label=f"{MODEL_INFO[key]['display']} ({auc:.3f})")
        ax.plot([0, 1], [0, 1], "k--", lw=0.8, alpha=0.5)
        ax.set_title(f"{c} - {CLASS_LONG[c][:34]}", fontsize=9)
        ax.set_xlabel("false positive rate"); ax.set_ylabel("true positive rate")
        ax.legend(fontsize=7, loc="lower right"); ax.grid(alpha=0.3)
    ax = axes[7]
    labels = [MODEL_INFO[k]["display"] for k in AVAILABLE_MODELS]
    aucs = [tab3_full.loc[tab3_full.model == l, "roc_auc_macro_ovr"].values[0] for l in labels]
    errs = [tab3_full.loc[tab3_full.model == l, "roc_auc_macro_ovr_sd"].values[0] for l in labels]
    ax.bar(range(len(labels)), aucs, yerr=np.nan_to_num(errs), capsize=4,
           color=colors[:len(labels)], edgecolor="black", linewidth=0.6)
    ax.set_xticks(range(len(labels)))
    ax.set_xticklabels(labels, rotation=25, ha="right", fontsize=8)
    ax.set_ylim(0.5, 1.0); ax.set_ylabel("macro OvR ROC-AUC")
    ax.set_title("Macro ROC-AUC (mean +/- SD over seeds)", fontsize=9); ax.grid(axis="y", alpha=0.3)
    plt.suptitle("Figure 2 - One-vs-rest ROC curves, HAM10000 test "
                 "(probabilities averaged over seeds)", fontsize=13, y=1.005)
    plt.tight_layout()
    plt.savefig(CFG.fig_dir / "figure2_roc_curves.png", dpi=300, bbox_inches="tight")
    plt.show()

In [ ]:
# ============================================================================
# Cell 10.5 - Figure 3: performance comparison with 95% CIs
# ============================================================================
if AVAILABLE_MODELS:
    metrics_show = ["accuracy", "balanced_accuracy", "macro_f1", "weighted_f1"]
    labels = [MODEL_INFO[k]["display"] for k in AVAILABLE_MODELS]
    fig, axes = plt.subplots(1, 3, figsize=(18, 5.2))

    ax = axes[0]
    w = 0.8 / len(metrics_show)
    x = np.arange(len(labels))
    for i, m in enumerate(metrics_show):
        vals = [tab3_full.loc[tab3_full.model == l, m].values[0] for l in labels]
        lo = [tab3_full.loc[tab3_full.model == l, f"{m}_ci_lo"].values[0] for l in labels]
        hi = [tab3_full.loc[tab3_full.model == l, f"{m}_ci_hi"].values[0] for l in labels]
        err = np.array([np.nan_to_num(np.array(vals) - np.array(lo)),
                        np.nan_to_num(np.array(hi) - np.array(vals))])
        ax.bar(x + i * w - 0.4 + w / 2, vals, w, yerr=err, capsize=3,
               label=m.replace("_", " "), edgecolor="black", linewidth=0.5)
    ax.set_xticks(x); ax.set_xticklabels(labels, rotation=20, ha="right", fontsize=8)
    ax.set_ylabel("score"); ax.set_ylim(0, 1.0); ax.legend(fontsize=8)
    ax.set_title(f"HAM10000 test, mean with {CFG.ci_level:.0%} CI"); ax.grid(axis="y", alpha=0.3)

    ax = axes[1]
    piv = pc_df.pivot(index="class", columns="model", values="f1").reindex(CLASSES)
    piv.plot(kind="bar", ax=ax, edgecolor="black", linewidth=0.5, width=0.8, legend=True)
    ax.set_ylabel("per-class F1"); ax.set_xlabel("")
    ax.set_title("Per-class F1 (mean over seeds)"); ax.legend(fontsize=7)
    ax.grid(axis="y", alpha=0.3); ax.tick_params(axis="x", rotation=0)

    ax = axes[2]
    for key in AVAILABLE_MODELS:
        vals = [PER_RUN_METRICS[f"{key}_seed{s}"]["macro_f1"] for s in CFG.seeds
                if f"{key}_seed{s}" in PER_RUN_METRICS]
        ax.scatter([MODEL_INFO[key]["display"]] * len(vals), vals, s=60, zorder=3)
    ax.set_ylabel("macro F1 per seed"); ax.set_title("Seed-level spread (stability)")
    ax.tick_params(axis="x", rotation=20); ax.grid(axis="y", alpha=0.3)
    plt.suptitle("Figure 3 - Performance comparison on HAM10000", fontsize=13, y=1.02)
    plt.tight_layout()
    plt.savefig(CFG.fig_dir / "figure3_performance_comparison.png", dpi=300, bbox_inches="tight")
    plt.show()

---
## 11. BCN20000 External Validation

**Experiment B.** The HAM10000-trained weights are applied to the external set **without any retraining,
fine-tuning, or threshold adjustment**. The label mapping frozen in Section 3.5 is re-verified by
hash before a single external image is loaded.

The comparison is deliberately like-for-like: the identical binary projection is applied to the
HAM10000 test set restricted to `{mel, nv}` (the *internal* binary reference) and to the external set restricted the same way — 2,179 BCN20000 images, 999 melanoma and 1,180 nevus (the
*external* set). Reported degradation is therefore

> `degradation(%) = 100 · (internal_binary − external) / internal_binary`

which isolates domain shift from the change of task granularity. Comparing 7-class HAM10000
accuracy against binary external accuracy — a common error in the cross-dataset literature — would
confound the two and is not done here.

In [ ]:
# ============================================================================
# Cell 11.1 - Verify the frozen mapping, then evaluate the external set
# ============================================================================
_check = hashlib.sha256(json.dumps(LABEL_MAPPING, sort_keys=True).encode()).hexdigest()[:16]
assert _check == MAPPING_HASH, (
    "The cross-dataset label mapping changed after it was frozen in Section 3.5. "
    "Post-hoc remapping invalidates external validation - aborting.")
print(f"Label mapping verified unchanged (SHA-256[:16] = {MAPPING_HASH}).")

EXT_PRED, EXT_METRICS, INTERNAL_BINARY = {}, {}, {}
PROJECTIONS = ["restricted", "marginal"]

def binary_metrics(y_true, score, threshold=0.5):
    y_pred = (score >= threshold).astype(int)
    cm = confusion_matrix(y_true, y_pred, labels=[0, 1])
    tn, fp, fn, tp = cm.ravel()
    out = {
        "accuracy": accuracy_score(y_true, y_pred),
        "balanced_accuracy": balanced_accuracy_score(y_true, y_pred),
        "macro_f1": f1_score(y_true, y_pred, average="macro", zero_division=0),
        "f1_melanoma": f1_score(y_true, y_pred, pos_label=1, zero_division=0),
        "sensitivity": tp / max(tp + fn, 1),
        "specificity": tn / max(tn + fp, 1),
        "precision_melanoma": tp / max(tp + fp, 1),
        "n": int(len(y_true)),
        "confusion_matrix": cm.tolist(),
    }
    out["roc_auc"] = (roc_auc_score(y_true, score) if len(np.unique(y_true)) == 2 else np.nan)
    return out

# ---- internal binary reference (HAM10000 test restricted to {mel, nv}) ------
mask_bin = test_df.label.isin(["mel", "nv"]).values
y_int = np.array([LABEL_MAPPING["ham10000_to_binary"][l]
                  for l in test_df.label.values[mask_bin]])
print(f"Internal binary reference: {mask_bin.sum()} HAM10000 test images "
      f"({int((y_int == 1).sum())} melanoma / {int((y_int == 0).sum())} nevus)")

for rid, d in TEST_PRED.items():
    for proj in PROJECTIONS:
        s = binary_scores(d["probs"][mask_bin], proj)
        INTERNAL_BINARY[(rid, proj)] = binary_metrics(y_int, s)

# ---- external evaluation ----------------------------------------------------
if EXT_AVAILABLE:
    ext_df = ext_df.copy()
    # ext_df stays complete and drives the 7-class evaluation. ext_bin_df is the
    # {mel, nv} subset and drives the binary task. Keeping them apart avoids a
    # NaN-laden `binary` column being mistaken for labels, and keeps the reported
    # sample sizes honest for each task.
    ext_bin_df = ext_df[ext_df.ext_label.isin(LABEL_MAPPING["ext_to_binary"])] \
                       .reset_index(drop=True).copy()
    ext_bin_df["binary"] = ext_bin_df["ext_label"].map(
        LABEL_MAPPING["ext_to_binary"]).astype(int)
    _n_held = len(ext_df) - len(ext_bin_df)
    if _n_held:
        print(f"  {_n_held} external images fall outside {{mel, nv}}; they are excluded from")
        print("  the binary task but retained for the 7-class evaluation.")
    print(f"{EXT_NAME} binary targets: {int((ext_bin_df.binary == 1).sum())} melanoma / "
          f"{int((ext_bin_df.binary == 0).sum())} nevus")
    with Timer("evaluation_external", TIMINGS, verbose=False):
        for key in AVAILABLE_MODELS:
            info = MODEL_INFO[key]
            _, eval_tf = build_transforms(info["mean"], info["std"], CFG.img_size)
            loader = make_loader(ext_bin_df, eval_tf, BATCH_SIZE * 2, False, 0, label_col="binary")
            for seed in CFG.seeds:
                rid = f"{key}_seed{seed}"
                if not (CFG.ckpt_dir / rid / "best.pt").exists():
                    continue
                model, _ = load_run_model(key, seed)
                ev = evaluate(model, loader, return_probs=True)
                EXT_PRED[rid] = {"key": key, "seed": seed, "y_true": ext_bin_df.binary.values,
                                 "probs7": ev["probs"], "image_id": ext_bin_df.image_id.values}
                np.savez_compressed(CFG.pred_dir / f"{rid}_external.npz",
                                    y_true=ext_bin_df.binary.values, probs7=ev["probs"],
                                    image_id=ext_bin_df.image_id.values)
                for proj in PROJECTIONS:
                    EXT_METRICS[(rid, proj)] = binary_metrics(
                        ext_bin_df.binary.values, binary_scores(ev["probs"], proj))
                m = EXT_METRICS[(rid, "restricted")]
                print(f"  {rid:<28} ext bAcc {m['balanced_accuracy']:.4f}  "
                      f"sens {m['sensitivity']:.4f}  spec {m['specificity']:.4f}  "
                      f"AUC {m['roc_auc']:.4f}")
                del model; gc.collect(); torch.cuda.empty_cache()
else:
    print("=" * 90)
    print(f"EXPERIMENT B SKIPPED - {EXT_NAME} is not available in this runtime.")
    print("No external-validation figures are produced. Table 4 will report N/A for every model.")
    print("This is a deliberate omission, not a missing result: cross-dataset numbers are never")
    print("estimated, imputed, or copied from the literature in this notebook.")
    print("=" * 90)

Label mapping verified unchanged (SHA-256[:16] = 8d75239e2426c3c1).
Internal binary reference: 1206 HAM10000 test images (167 melanoma / 1039 nevus)
  1479 external images fall outside {mel, nv}; they are excluded from
  the binary task but retained for the 7-class evaluation.
BCN20000 binary targets: 999 melanoma / 1180 nevus
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed42         ext bAcc 0.7098  sens 0.8288  spec 0.5907  AUC 0.8245
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed123        ext bAcc 0.7460  sens 0.6326  spec 0.8593  AUC 0.8112
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed2024       ext bAcc 0.7235  sens 0.5325  spec 0.9144  AUC 0.8174
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196

In [ ]:
# ============================================================================
# Cell 11.2 - Table 4: external validation and performance degradation
# ============================================================================
EXT_METRIC_KEYS = ["accuracy", "balanced_accuracy", "macro_f1", "sensitivity", "specificity", "roc_auc"]
rows4 = []
for key in AVAILABLE_MODELS:
    rids = [f"{key}_seed{s}" for s in CFG.seeds if f"{key}_seed{s}" in TEST_PRED]
    row = {"model": MODEL_INFO[key]["display"]}
    for m in EXT_METRIC_KEYS:
        iv = [INTERNAL_BINARY[(r, "restricted")][m] for r in rids]
        mi, si, ci, _ = mean_sd_ci(iv, CFG.ci_level)
        row[f"internal_{m}"] = mi
        row[f"internal_{m}_str"] = f"{mi:.4f} +/- {si:.4f}" if np.isfinite(si) else f"{mi:.4f}"
        if EXT_AVAILABLE:
            ev_ = [EXT_METRICS[(r, "restricted")][m] for r in rids if (r, "restricted") in EXT_METRICS]
            me, se, ce, _ = mean_sd_ci(ev_, CFG.ci_level)
            row[f"ext_{m}"] = me
            row[f"ext_{m}_str"] = (f"{me:.4f} +/- {se:.4f} [{ce[0]:.4f}, {ce[1]:.4f}]"
                                   if np.isfinite(se) else f"{me:.4f}")
            row[f"degradation_{m}_pct"] = (100 * (mi - me) / mi) if (np.isfinite(mi) and mi > 0) else np.nan
        else:
            row[f"ext_{m}"] = np.nan
            row[f"ext_{m}_str"] = f"N/A ({EXT_NAME} unavailable)"
            row[f"degradation_{m}_pct"] = np.nan
    # secondary projection, reported as a sensitivity analysis
    if EXT_AVAILABLE:
        sec = [EXT_METRICS[(r, "marginal")]["balanced_accuracy"] for r in rids
               if (r, "marginal") in EXT_METRICS]
        row["ext_bacc_marginal_projection"] = float(np.mean(sec)) if sec else np.nan
    rows4.append(row)
for key, err in EXCLUDED_MODELS.items():
    rows4.append({"model": f"{key} (EXCLUDED)",
                  **{f"ext_{m}_str": "EXCLUDED" for m in EXT_METRIC_KEYS}})
tab4_full = pd.DataFrame(rows4)

show_cols = ["model"] + [f"internal_{m}_str" for m in ["balanced_accuracy", "sensitivity", "specificity", "roc_auc"]] \
            + [f"ext_{m}_str" for m in EXT_METRIC_KEYS] + ["degradation_balanced_accuracy_pct"]
show_cols = [c for c in show_cols if c in tab4_full.columns]
tab4 = tab4_full[show_cols].copy()
tab4.columns = [c.replace("_str", "").replace("internal_", "HAM(bin) ")
                 .replace("ext_", f"{EXT_NAME} ").replace("_", " ") for c in tab4.columns]

print("=" * 160)
print(f"TABLE 4 - External validation on {EXT_NAME} (binary melanoma vs nevus, NO retraining)")
print(f"          Internal reference = HAM10000 test restricted to {{mel, nv}} "
      f"(n={int(mask_bin.sum())}); external = {EXT_NAME} (n={len(ext_bin_df) if EXT_AVAILABLE else 0})")
print("=" * 160)
print(tab4.to_string(index=False, float_format=lambda v: f"{v:8.2f}"))
print("=" * 160)
if EXT_AVAILABLE:
    print(f"Positive degradation = the model performs WORSE on {EXT_NAME} than on the internal task.")
    print("A negative value means it performs better externally, which usually reflects the")
    print("easier melanoma/nevus contrast rather than better generalisation.")
save_table(tab4, "table4_external_validation",
           f"Table 4 - {EXT_NAME} external validation")
save_table(tab4_full, "table4_external_validation_full")

if EXT_AVAILABLE:
    fig, axes = plt.subplots(1, 3, figsize=(17, 4.8))
    labels = [MODEL_INFO[k]["display"] for k in AVAILABLE_MODELS]
    x = np.arange(len(labels))
    ax = axes[0]
    ax.bar(x - 0.2, tab4_full.internal_balanced_accuracy[:len(labels)], 0.4,
           label="HAM10000 (binary subset)", edgecolor="black", linewidth=0.5)
    ax.bar(x + 0.2, tab4_full.ext_balanced_accuracy[:len(labels)], 0.4,
           label=f"{EXT_NAME} (external)", edgecolor="black", linewidth=0.5)
    ax.set_xticks(x); ax.set_xticklabels(labels, rotation=20, ha="right", fontsize=8)
    ax.set_ylabel("balanced accuracy"); ax.legend(fontsize=8); ax.grid(axis="y", alpha=0.3)
    ax.set_title("Internal vs external")

    ax = axes[1]
    deg = tab4_full.degradation_balanced_accuracy_pct[:len(labels)]
    ax.bar(x, deg, color=["#c1666b" if d > 0 else "#5a8f5a" for d in deg],
           edgecolor="black", linewidth=0.5)
    ax.axhline(0, color="black", lw=0.8)
    ax.set_xticks(x); ax.set_xticklabels(labels, rotation=20, ha="right", fontsize=8)
    ax.set_ylabel("degradation (%)"); ax.set_title(f"Balanced-accuracy degradation on {EXT_NAME}")
    ax.grid(axis="y", alpha=0.3)

    ax = axes[2]
    for i, key in enumerate(AVAILABLE_MODELS):
        rids = [f"{key}_seed{s}" for s in CFG.seeds if f"{key}_seed{s}" in EXT_PRED]
        sc = np.mean([binary_scores(EXT_PRED[r]["probs7"], "restricted") for r in rids], axis=0)
        fpr, tpr, _ = roc_curve(ext_bin_df.binary.values, sc)
        ax.plot(fpr, tpr, lw=1.6,
                label=f"{labels[i]} ({roc_auc_score(ext_bin_df.binary.values, sc):.3f})")
    ax.plot([0, 1], [0, 1], "k--", lw=0.8, alpha=0.5)
    ax.set_xlabel("false positive rate"); ax.set_ylabel("true positive rate")
    ax.set_title(f"{EXT_NAME} ROC (melanoma vs nevus)"); ax.legend(fontsize=7, loc="lower right")
    ax.grid(alpha=0.3)
    plt.suptitle(f"{EXT_NAME} external validation", fontsize=13, y=1.03)
    plt.tight_layout()
    plt.savefig(CFG.fig_dir / "figure4a_external_validation.png", dpi=300, bbox_inches="tight")
    plt.show()

---
## 12. Statistical Testing

### 12.1 Why McNemar

Every model is evaluated on the **same** test images with the **same** split, so the predictions
are paired. McNemar's test is the standard instrument for comparing two classifiers on paired
nominal outcomes: it conditions on the discordant pairs — the cases where exactly one model is
correct — and ignores the (many) cases where both agree, which carry no information about a
difference.

For a pair of models the 2x2 contingency table of correctness is

| | B correct | B wrong |
|---|---|---|
| **A correct** | a | b |
| **A wrong** | c | d |

and the test statistic depends only on `b` and `c`. We use the **exact binomial** version when
`b + c < 25` and the chi-square version with continuity correction otherwise, because the
chi-square approximation is unreliable for few discordant pairs.

### 12.2 Multiplicity

Six pairwise comparisons are made per seed. Raw p-values are corrected with the **Holm–Bonferroni**
step-down procedure, which controls the family-wise error rate without assuming independence and
is uniformly more powerful than plain Bonferroni. Two families are reported:

* **Within-seed family** (6 tests) — the primary analysis, repeated for each seed.
* **Global family** (all model pairs x all seeds) — a stricter secondary analysis.

A difference is called **significant** only if the *corrected* p-value is below 0.05. A model is
described as better than another only if the difference is significant **in the same direction in
all seeds** — numerical superiority in a single run is explicitly not sufficient.

In [ ]:
# ============================================================================
# Cell 12.1 - Table 5: pairwise McNemar tests with Holm correction
# ============================================================================
from itertools import combinations

def mcnemar_pair(correct_a: np.ndarray, correct_b: np.ndarray, exact_thr: int):
    b = int(np.sum(correct_a & ~correct_b))
    c = int(np.sum(~correct_a & correct_b))
    table = [[int(np.sum(correct_a & correct_b)), b], [c, int(np.sum(~correct_a & ~correct_b))]]
    use_exact = (b + c) < exact_thr
    res = mcnemar(np.array(table), exact=use_exact, correction=not use_exact)
    return {"b_only_A_correct": b, "c_only_B_correct": c, "n_discordant": b + c,
            "test": "exact binomial" if use_exact else "chi2 (continuity corrected)",
            "statistic": float(res.statistic), "p_raw": float(res.pvalue)}

stat_rows = []
if len(AVAILABLE_MODELS) >= 2:
    with Timer("statistical_testing", TIMINGS, verbose=False):
        for seed in CFG.seeds:
            entries = []
            for ka, kb in combinations(AVAILABLE_MODELS, 2):
                ra, rb = f"{ka}_seed{seed}", f"{kb}_seed{seed}"
                if ra not in TEST_PRED or rb not in TEST_PRED:
                    continue
                ca = TEST_PRED[ra]["y_pred"] == TEST_PRED[ra]["y_true"]
                cb = TEST_PRED[rb]["y_pred"] == TEST_PRED[rb]["y_true"]
                assert np.array_equal(TEST_PRED[ra]["y_true"], TEST_PRED[rb]["y_true"]), \
                    "paired test requires identical test targets"
                r = mcnemar_pair(ca, cb, CFG.mcnemar_exact_threshold)
                r.update(seed=seed, model_A=MODEL_INFO[ka]["display"],
                         model_B=MODEL_INFO[kb]["display"], key_A=ka, key_B=kb,
                         acc_A=float(ca.mean()), acc_B=float(cb.mean()))
                entries.append(r)
            if entries:
                rej, p_adj, _, _ = multipletests([e["p_raw"] for e in entries], alpha=0.05,
                                                 method="holm")
                for e, pa, rj in zip(entries, p_adj, rej):
                    e["p_holm_within_seed"] = float(pa)
                    e["significant_within_seed"] = bool(rj)
                    e["direction"] = ("A > B" if e["acc_A"] > e["acc_B"]
                                      else "B > A" if e["acc_B"] > e["acc_A"] else "tie")
                stat_rows.extend(entries)

if stat_rows:
    rej_g, p_g, _, _ = multipletests([e["p_raw"] for e in stat_rows], alpha=0.05, method="holm")
    for e, pa, rj in zip(stat_rows, p_g, rej_g):
        e["p_holm_global"] = float(pa)
        e["significant_global"] = bool(rj)

tab5_full = pd.DataFrame(stat_rows)
if len(tab5_full):
    tab5 = tab5_full[["seed", "model_A", "model_B", "acc_A", "acc_B", "b_only_A_correct",
                      "c_only_B_correct", "n_discordant", "test", "p_raw",
                      "p_holm_within_seed", "significant_within_seed",
                      "p_holm_global", "significant_global", "direction"]]
    print("=" * 170)
    print("TABLE 5 - Pairwise McNemar tests on paired HAM10000 test predictions "
          "(Holm-corrected, alpha = 0.05)")
    print("=" * 170)
    print(tab5.to_string(index=False, float_format=lambda v: f"{v:.5f}"))
    print("=" * 170)
    save_table(tab5, "table5_statistical_significance",
               "Table 5 - Pairwise McNemar tests with Holm correction")

    print(f"\nCONSENSUS ACROSS SEEDS (a claim of superiority requires all "
          f"{len(CFG.seeds)} seeds to agree):")
    cons_rows = []
    for ka, kb in combinations(AVAILABLE_MODELS, 2):
        sub = tab5_full[(tab5_full.key_A == ka) & (tab5_full.key_B == kb)]
        if not len(sub):
            continue
        n_sig = int(sub.significant_within_seed.sum())
        dirs = set(sub.loc[sub.significant_within_seed, "direction"])
        verdict = ("no significant difference" if n_sig == 0 else
                   f"significant in {n_sig}/{len(sub)} seeds - INCONCLUSIVE"
                   if n_sig < len(sub) or len(dirs) > 1 else
                   f"consistently significant, {dirs.pop()}")
        cons_rows.append({"pair": f"{MODEL_INFO[ka]['display']} vs {MODEL_INFO[kb]['display']}",
                          "seeds_significant": f"{n_sig}/{len(sub)}",
                          "median_p_holm": float(sub.p_holm_within_seed.median()),
                          "verdict": verdict})
    cons_df = pd.DataFrame(cons_rows)
    print(cons_df.to_string(index=False, float_format=lambda v: f"{v:.5f}"))
    save_table(cons_df, "table5b_significance_consensus", "Cross-seed significance consensus")
else:
    cons_df = pd.DataFrame(columns=["pair", "seeds_significant", "median_p_holm", "verdict"])
    print("Fewer than two models available - no pairwise statistical testing performed.")

### 12.2 Paired lesion-level bootstrap on the primary metric

Section 12.1 tests **overall accuracy**. On HAM10000 that is dominated by `nv`, which is about
two thirds of the data, so a model can win the McNemar test while being worse at exactly the
classes that matter. The reported primary metrics are macro-F1 and balanced accuracy — and
McNemar cannot test either of them, because neither decomposes into per-sample wins and losses.

This cell closes that gap with a **paired bootstrap** on the stored test predictions. Three
properties make it valid:

- **Paired** — every resample draws one index set and scores *all* models on it, so the
  difference is computed on identical data, exactly as McNemar's pairing requires.
- **Clustered by lesion** — resampling is over `group_id`, not over images. The split itself is
  lesion-disjoint because images of one lesion are not independent; resampling at image level
  would contradict that and understate the uncertainty. The resampling unit matches the split unit.
- **Zero GPU cost** — it reads `TEST_PRED`, which already exists. Nothing is retrained.

Holm correction is applied across the pairs within each seed, matching Section 12.1. A
superiority claim still requires agreement across all seeds.

In [ ]:
# ============================================================================
# Cell 12.2 - Paired lesion-level bootstrap on macro-F1 and balanced accuracy
# ============================================================================
N_BOOT = 2000
BOOT_SEED = 20240101          # fixed and independent of the model seeds

def _fast_cm(y, p, k=NUM_CLASSES):
    return np.bincount(y * k + p, minlength=k * k).reshape(k, k)

def macro_f1_fast(y, p, k=NUM_CLASSES):
    cm = _fast_cm(y, p, k)
    tp = np.diag(cm).astype(float)
    denom = 2 * tp + (cm.sum(0) - tp) + (cm.sum(1) - tp)
    return float(np.mean(np.divide(2 * tp, denom, out=np.zeros(k), where=denom > 0)))

def balanced_acc_fast(y, p, k=NUM_CLASSES):
    cm = _fast_cm(y, p, k)
    sup = cm.sum(1)
    rec = np.divide(np.diag(cm).astype(float), sup, out=np.zeros(k), where=sup > 0)
    return float(rec[sup > 0].mean()) if (sup > 0).any() else float("nan")

METRIC_FNS = {"macro_f1": macro_f1_fast, "balanced_accuracy": balanced_acc_fast}

def paired_cluster_bootstrap(pred_a, pred_b, y_true, groups, metric_fn,
                             n_boot=N_BOOT, seed=BOOT_SEED):
    """Bootstrap the paired difference metric(A) - metric(B), resampling LESIONS."""
    _, inv = np.unique(groups, return_inverse=True)
    n_groups = inv.max() + 1
    idx_by_group = [np.where(inv == g)[0] for g in range(n_groups)]
    rng = np.random.default_rng(seed)
    diffs = np.empty(n_boot)
    for b in range(n_boot):
        pick = rng.integers(0, n_groups, n_groups)
        idx = np.concatenate([idx_by_group[j] for j in pick])
        diffs[b] = metric_fn(y_true[idx], pred_a[idx]) - metric_fn(y_true[idx], pred_b[idx])
    obs = metric_fn(y_true, pred_a) - metric_fn(y_true, pred_b)
    lo, hi = np.percentile(diffs, [2.5, 97.5])
    # two-sided bootstrap p, clamped to [0, 1] (an exactly-zero difference gives p = 1)
    p_val = min(1.0, 2.0 * min(float((diffs <= 0).mean()), float((diffs >= 0).mean())))
    return {"observed_diff": float(obs), "ci_low": float(lo), "ci_high": float(hi),
            "p_raw": p_val, "n_boot": int(n_boot),
            "ci_excludes_zero": bool(lo > 0 or hi < 0)}

# lesion groups for the test split, aligned to the prediction order
_test_groups = test_df.group_id.values
assert len(_test_groups) == len(test_df), "group vector must align with test_df"

boot_rows = []
if len(AVAILABLE_MODELS) >= 2 and TEST_PRED:
    print("=" * 150)
    print(f"TABLE 5c - Paired lesion-level bootstrap ({N_BOOT} resamples over "
          f"{len(np.unique(_test_groups))} test lesions, seed {BOOT_SEED})")
    print("  Resampling unit = lesion, matching the lesion-disjoint split. No GPU used.")
    print("=" * 150)
    with Timer("paired_bootstrap", TIMINGS, verbose=False):
        for metric_name, fn in METRIC_FNS.items():
            for seed in CFG.seeds:
                entries = []
                for ka, kb in combinations(AVAILABLE_MODELS, 2):
                    ra, rb = f"{ka}_seed{seed}", f"{kb}_seed{seed}"
                    if ra not in TEST_PRED or rb not in TEST_PRED:
                        continue
                    y_true = TEST_PRED[ra]["y_true"]
                    assert np.array_equal(y_true, TEST_PRED[rb]["y_true"]), \
                        "paired bootstrap requires identical test targets"
                    r = paired_cluster_bootstrap(TEST_PRED[ra]["y_pred"],
                                                 TEST_PRED[rb]["y_pred"],
                                                 y_true, _test_groups, fn)
                    r.update(metric=metric_name, seed=seed,
                             model_A=MODEL_INFO[ka]["display"],
                             model_B=MODEL_INFO[kb]["display"], key_A=ka, key_B=kb)
                    entries.append(r)
                if entries:
                    rej, p_adj, _, _ = multipletests([e["p_raw"] for e in entries],
                                                     alpha=0.05, method="holm")
                    for e, pa, rj in zip(entries, p_adj, rej):
                        e["p_holm_within_seed"] = float(pa)
                        e["significant_within_seed"] = bool(rj)
                    boot_rows.extend(entries)

boot_df = pd.DataFrame(boot_rows)
if len(boot_df):
    show = boot_df[["metric", "seed", "model_A", "model_B", "observed_diff", "ci_low",
                    "ci_high", "ci_excludes_zero", "p_raw", "p_holm_within_seed",
                    "significant_within_seed"]]
    print(show.to_string(index=False, float_format=lambda v: f"{v:+.5f}"))
    print("=" * 150)
    save_table(show, "table5c_paired_bootstrap",
               "Table 5c - Paired lesion-level bootstrap on the primary metrics")

    print("\nCONSENSUS on the PRIMARY metric (macro-F1), all seeds must agree:")
    prim = boot_df[boot_df.metric == "macro_f1"]
    rows = []
    for ka, kb in combinations(AVAILABLE_MODELS, 2):
        sub = prim[(prim.key_A == ka) & (prim.key_B == kb)]
        if not len(sub):
            continue
        n_sig = int(sub.significant_within_seed.sum())
        dirs = {"A > B" if d > 0 else "B > A"
                for d in sub.loc[sub.significant_within_seed, "observed_diff"]}
        verdict = ("no significant difference in macro-F1" if n_sig == 0 else
                   f"significant in {n_sig}/{len(sub)} seeds - INCONCLUSIVE"
                   if n_sig < len(sub) or len(dirs) > 1 else
                   f"consistently significant, {dirs.pop()}")
        rows.append({"pair": f"{MODEL_INFO[ka]['display']} vs {MODEL_INFO[kb]['display']}",
                     "mean_diff_macro_f1": float(sub.observed_diff.mean()),
                     "seeds_significant": f"{n_sig}/{len(sub)}", "verdict": verdict})
    boot_cons = pd.DataFrame(rows)
    print(boot_cons.to_string(index=False, float_format=lambda v: f"{v:+.5f}"))
    save_table(boot_cons, "table5d_bootstrap_consensus",
               "Cross-seed consensus on macro-F1 (paired bootstrap)")
    print("\nRead Table 5 (accuracy, McNemar) and Table 5c (macro-F1, bootstrap) together.")
    print("Where they disagree, the primary metric governs: overall accuracy on HAM10000 is")
    print("dominated by the nevus class and is not the quantity this benchmark reports.")
else:
    boot_cons = pd.DataFrame(columns=["pair", "mean_diff_macro_f1", "seeds_significant", "verdict"])
    print("Paired bootstrap skipped - fewer than two models with stored predictions.")


### 12.3 Calibration

Accuracy says whether the top-1 label is right; it says nothing about whether a model's confidence
can be trusted. For a triage-framed task that is a separate and relevant property, and it is a
different axis from macro-F1 — a model can rank well and still be badly overconfident.

This costs **no GPU time at all**: the full softmax output of every run is already stored in
`results/predictions/*.npz`. The cell reports expected calibration error (ECE, 15 equal-width
confidence bins), maximum calibration error, Brier score, and mean confidence minus accuracy
(positive = overconfident), and draws reliability diagrams.

Note that these models are trained with **class-weighted** cross-entropy, which deliberately
distorts the predicted probabilities away from the empirical class frequencies. Some
miscalibration is therefore expected by construction and should be described that way rather
than as a defect of any architecture.

In [ ]:
# ============================================================================
# Cell 12.3 - Calibration from stored probabilities (zero GPU cost)
# ============================================================================
N_BINS = 15

def calibration_stats(probs: np.ndarray, y_true: np.ndarray, n_bins: int = N_BINS) -> dict:
    conf = probs.max(axis=1)
    pred = probs.argmax(axis=1)
    correct = (pred == y_true).astype(float)
    edges = np.linspace(0.0, 1.0, n_bins + 1)
    b_idx = np.clip(np.digitize(conf, edges[1:-1], right=False), 0, n_bins - 1)
    ece = mce = 0.0
    bins = []
    for b in range(n_bins):
        sel = b_idx == b
        if not sel.any():
            bins.append({"bin": b, "lo": edges[b], "hi": edges[b + 1], "n": 0,
                         "acc": np.nan, "conf": np.nan})
            continue
        acc_b, conf_b, w = correct[sel].mean(), conf[sel].mean(), sel.mean()
        gap = abs(acc_b - conf_b)
        ece += w * gap
        mce = max(mce, gap)
        bins.append({"bin": b, "lo": edges[b], "hi": edges[b + 1], "n": int(sel.sum()),
                     "acc": float(acc_b), "conf": float(conf_b)})
    onehot = np.zeros_like(probs)
    onehot[np.arange(len(y_true)), y_true] = 1.0
    brier = float(np.mean(np.sum((probs - onehot) ** 2, axis=1)))
    return {"ece": float(ece), "mce": float(mce), "brier_multiclass": brier,
            "mean_confidence": float(conf.mean()), "accuracy": float(correct.mean()),
            "overconfidence": float(conf.mean() - correct.mean()), "bins": bins}

cal_rows, cal_bins = [], {}
for key in AVAILABLE_MODELS:
    for seed in CFG.seeds:
        rid = f"{key}_seed{seed}"
        if rid not in TEST_PRED:
            continue
        st = calibration_stats(TEST_PRED[rid]["probs"], TEST_PRED[rid]["y_true"])
        cal_bins[rid] = st.pop("bins")
        cal_rows.append({"model": MODEL_INFO[key]["display"], "key": key, "seed": seed, **st})

cal_df = pd.DataFrame(cal_rows)
if len(cal_df):
    agg = cal_df.groupby("model").agg(
        ece_mean=("ece", "mean"), ece_sd=("ece", "std"),
        mce_mean=("mce", "mean"), brier_mean=("brier_multiclass", "mean"),
        mean_conf=("mean_confidence", "mean"), accuracy=("accuracy", "mean"),
        overconfidence=("overconfidence", "mean")).reset_index()
    print("=" * 130)
    print(f"TABLE 8 - Calibration on the HAM10000 test set "
          f"({N_BINS} bins, mean over {len(CFG.seeds)} seeds, no GPU used)")
    print("=" * 130)
    print(agg.to_string(index=False, float_format=lambda v: f"{v:.4f}"))
    print("=" * 130)
    print("Positive `overconfidence` = mean confidence exceeds accuracy.")
    print("Class-weighted cross-entropy intentionally shifts predicted probabilities away from")
    print("the empirical class frequencies, so some miscalibration is expected by construction.")
    save_table(agg, "table8_calibration", "Table 8 - Calibration (ECE, MCE, Brier)")
    save_table(cal_df, "table8_calibration_full")

    n = len(agg)
    fig, axes = plt.subplots(1, n, figsize=(4.0 * n, 4.0), squeeze=False)
    for ax, (_, row) in zip(axes[0], agg.iterrows()):
        key = cal_df[cal_df.model == row.model].key.iloc[0]
        rid = f"{key}_seed{CFG.seeds[0]}"
        bd = pd.DataFrame(cal_bins[rid])
        bd = bd[bd.n > 0]
        ax.plot([0, 1], [0, 1], "k--", lw=1, alpha=0.6, label="perfect calibration")
        ax.plot(bd.conf, bd.acc, "o-", color="#2b6cb0", lw=1.6, ms=4, label="observed")
        ax.bar(bd.conf, bd.acc - bd.conf, bottom=bd.conf, width=0.045,
               color="#c1666b", alpha=0.35, edgecolor="none", label="gap")
        ax.set_xlim(0, 1); ax.set_ylim(0, 1)
        ax.set_xlabel("confidence"); ax.set_ylabel("accuracy")
        ax.set_title(f"{row.model}\nECE = {row.ece_mean:.4f}", fontsize=10)
        ax.grid(alpha=0.25)
    axes[0][0].legend(fontsize=7, loc="upper left")
    fig.suptitle(f"Figure 6 - Reliability diagrams, HAM10000 test (seed {CFG.seeds[0]})",
                 fontsize=12)
    fig.tight_layout()
    fig.savefig(CFG.fig_dir / "figure6_calibration.png", dpi=300, bbox_inches="tight")
    plt.close(fig)
    print(f"Figure 6 -> {CFG.fig_dir}/figure6_calibration.png")
else:
    print("Calibration skipped - no stored test predictions.")


---
## 13. Corruption Robustness

**Experiment C.** Robustness is probed with corruptions that mimic realistic dermoscopy
acquisition problems, applied **on the fly** to the already-held-out test images. No corrupted
dataset is materialised on disk, and **no model is retrained or recalibrated**.

| Corruption | Severities | What it simulates |
|---|---|---|
| Brightness | x0.7, x1.3 | exposure error, polarised vs non-polarised capture |
| Contrast | x0.7, x1.3 | device/display calibration differences |
| Gaussian noise | sigma = 0.05, 0.10 | low-light sensor noise |
| Gaussian blur | radius = 1.0, 2.0 | defocus, contact-gel smear |
| JPEG compression | quality 50, 30 | lossy storage/transmission in clinical PACS |

Every corruption is applied **after** the deterministic resize/centre-crop and **before**
normalisation, so the corruption acts on the pixel values the model would actually receive. For
each model we report clean performance, corrupted performance, and the relative degradation

> `degradation(%) = 100 · (clean − corrupted) / clean`

aggregated over the robustness seeds (`CFG.robustness_seeds`). Cost is low because this is inference only.

In [ ]:
# ============================================================================
# Cell 13.1 - Corruption transforms, applied to a decoded-tensor cache
# ============================================================================
# The previous version rebuilt a DataLoader for every (model, seed, corruption) pair:
# 11 conditions x 12 runs x 2 datasets = 264 DataLoader constructions, each spawning and
# tearing down worker processes, and each re-reading and re-decoding the whole test set
# from disk. That re-did identical work 132 times: the resize/centre-crop and the
# corruption itself depend only on the image and the corruption, never on the model.
#
# Instead the test set is decoded and geometrically preprocessed ONCE into a uint8 array,
# each corruption is materialised ONCE, and every model then reads from RAM. Only the
# per-model normalisation differs, and that is a cheap GPU op.
#
# Corruptions are defined in 8-bit image space, which is what a real corrupted image is;
# results are identical in kind to the PIL pipeline and identical for every model, so the
# comparison remains fair.

CORRUPTIONS = [
    ("clean",           None),
    ("brightness_0.7",  ("brightness", 0.7)),
    ("brightness_1.3",  ("brightness", 1.3)),
    ("contrast_0.7",    ("contrast", 0.7)),
    ("contrast_1.3",    ("contrast", 1.3)),
    ("gauss_noise_005", ("noise", 0.05)),
    ("gauss_noise_010", ("noise", 0.10)),
    ("gauss_blur_1.0",  ("blur", 1.0)),
    ("gauss_blur_2.0",  ("blur", 2.0)),
    ("jpeg_q50",        ("jpeg", 50)),
    ("jpeg_q30",        ("jpeg", 30)),
]
assert [c for c, _ in CORRUPTIONS if c != "clean"] == CORRUPTION_NAMES, \
    "CORRUPTION_NAMES (Section 2.5, used for the budget projection) is out of sync"

def decode_eval_cache(df, img_size: int) -> np.ndarray:
    """Decode + Resize(256/224) + CenterCrop once -> uint8 [N, H, W, 3]."""
    geom = T.Compose([T.Resize(int(img_size * 256 / 224),
                               interpolation=T.InterpolationMode.BICUBIC),
                      T.CenterCrop(img_size)])
    paths = df["path"].tolist()
    out = np.empty((len(paths), img_size, img_size, 3), dtype=np.uint8)
    def _one(i):
        with Image.open(paths[i]) as im:
            out[i] = np.asarray(geom(im.convert("RGB")), dtype=np.uint8)
    with ThreadPoolExecutor(max_workers=CFG.num_workers) as ex:
        list(tqdm(ex.map(_one, range(len(paths))), total=len(paths),
                  desc="decoding eval cache", leave=False))
    return out

def apply_corruption(base: np.ndarray, corruption, noise_seed: int = 12345) -> np.ndarray:
    """Apply one corruption to a uint8 [N, H, W, 3] cache. Deterministic."""
    if corruption is None:
        return base
    kind, sev = corruption
    if kind == "brightness":
        # PIL ImageEnhance.Brightness blends with black -> a plain multiply.
        return np.clip(base.astype(np.float32) * sev, 0, 255).astype(np.uint8)
    if kind == "contrast":
        # PIL ImageEnhance.Contrast blends with a flat grey equal to the mean of the
        # L-converted image, rounded to an integer. Replicated exactly, per image.
        f = base.astype(np.float32)
        lum = (f[..., 0] * 299 + f[..., 1] * 587 + f[..., 2] * 114) / 1000.0
        grey = np.round(lum.reshape(len(base), -1).mean(axis=1)).astype(np.float32)
        grey = grey.reshape(-1, 1, 1, 1)
        return np.clip(grey + sev * (f - grey), 0, 255).astype(np.uint8)
    if kind == "noise":
        rng = np.random.default_rng(noise_seed)
        n = rng.standard_normal(base.shape, dtype=np.float32) * (sev * 255.0)
        return np.clip(base.astype(np.float32) + n, 0, 255).astype(np.uint8)
    if kind in ("blur", "jpeg"):
        out = np.empty_like(base)
        def _one(i):
            im = Image.fromarray(base[i])
            if kind == "blur":
                im = im.filter(ImageFilter.GaussianBlur(radius=sev))
            else:
                buf = io.BytesIO()
                im.save(buf, format="JPEG", quality=int(sev))
                buf.seek(0)
                im = Image.open(buf).convert("RGB")
            out[i] = np.asarray(im, dtype=np.uint8)
        with ThreadPoolExecutor(max_workers=CFG.num_workers) as ex:
            list(ex.map(_one, range(len(base))))
        return out
    raise ValueError(f"unknown corruption {kind!r}")

@torch.no_grad()
def evaluate_cached(model, arr_u8: np.ndarray, mean, std, batch: int) -> np.ndarray:
    """Softmax probabilities for a uint8 cache. Normalisation happens on the GPU."""
    model.eval()
    m = torch.tensor(mean, device=DEVICE, dtype=torch.float32).view(1, 3, 1, 1) * 255.0
    s = torch.tensor(std, device=DEVICE, dtype=torch.float32).view(1, 3, 1, 1) * 255.0
    probs = []
    for i in range(0, len(arr_u8), batch):
        x = torch.from_numpy(arr_u8[i:i + batch]).to(DEVICE, non_blocking=True)
        x = x.permute(0, 3, 1, 2).float().sub_(m).div_(s)
        with torch.autocast("cuda", dtype=AMP_DTYPE, enabled=CFG.amp):
            out = model(x)
        probs.append(torch.softmax(out.float(), dim=1).cpu())
    return torch.cat(probs).numpy()

# --- verify the cached path reproduces the DataLoader path --------------------
# A silent mismatch here would invalidate every robustness number, so it is checked
# rather than assumed.
_probe = test_df.head(8)
_cache_probe = decode_eval_cache(_probe, CFG.img_size)
_, _eval_tf = build_transforms(IMAGENET_MEAN, IMAGENET_STD, CFG.img_size)
_ref = torch.stack([_eval_tf(Image.open(p).convert("RGB")) for p in _probe.path])
_got = torch.from_numpy(_cache_probe).permute(0, 3, 1, 2).float().div(255.0)
_got = (_got - torch.tensor(IMAGENET_MEAN).view(1, 3, 1, 1)) / torch.tensor(IMAGENET_STD).view(1, 3, 1, 1)
_max_dev = (_ref - _got).abs().max().item()
record("cached eval path matches DataLoader path", _max_dev < 0.02,
       f"max |deviation| = {_max_dev:.5f} over an 8-image probe (8-bit quantisation only)")
if _max_dev >= 0.02:
    raise RuntimeError(
        f"Cached evaluation path deviates from the reference DataLoader path by "
        f"{_max_dev:.5f}. Every robustness number would be invalid - aborting.")
print(f"Corruption cache verified against the reference pipeline: max deviation {_max_dev:.5f}")
del _probe, _cache_probe, _ref, _got


In [ ]:
# ============================================================================
# Cell 13.2 - Table 6: robustness under corruption (decode once, evaluate many)
# ============================================================================
ROBUST_ON_EXT = EXT_AVAILABLE
rob_rows = []

with Timer("robustness_evaluation", TIMINGS, verbose=False):
    GUARD.authorise("corruption robustness (HAM10000 test)")
    print("Materialising corrupted copies once (shared by every model and seed)...")
    t_cache = time.perf_counter()
    ham_base = decode_eval_cache(test_df, CFG.img_size)
    ham_sets = {name: apply_corruption(ham_base, corr) for name, corr in CORRUPTIONS}
    n_bytes = sum(a.nbytes for a in ham_sets.values())
    if ROBUST_ON_EXT:
        ext_base = decode_eval_cache(ext_bin_df, CFG.img_size)
        ext_sets = {name: apply_corruption(ext_base, corr) for name, corr in CORRUPTIONS}
        n_bytes += sum(a.nbytes for a in ext_sets.values())
    print(f"  {len(CORRUPTIONS)} conditions cached in {fmt_hms(time.perf_counter() - t_cache)} "
          f"({n_bytes / 1024**3:.2f} GiB RAM); decoding is now done for the whole section.")

    for key in AVAILABLE_MODELS:
        info = MODEL_INFO[key]
        for seed in CFG.robustness_seeds:
            rid = f"{key}_seed{seed}"
            if not (CFG.ckpt_dir / rid / "best.pt").exists():
                continue
            model, _ = load_run_model(key, seed)
            for cname, _corr in CORRUPTIONS:
                probs = evaluate_cached(model, ham_sets[cname], info["mean"], info["std"],
                                        BATCH_SIZE * 2)
                m = compute_metrics(test_df.label_idx.values, probs.argmax(1), probs,
                                    class_names=CLASSES)
                rob_rows.append({"dataset": "HAM10000-test", "model": info["display"],
                                 "key": key, "seed": seed, "corruption": cname,
                                 "accuracy": m["accuracy"],
                                 "balanced_accuracy": m["balanced_accuracy"],
                                 "macro_f1": m["macro_f1"]})
                if ROBUST_ON_EXT:
                    p2 = evaluate_cached(model, ext_sets[cname], info["mean"], info["std"],
                                         BATCH_SIZE * 2)
                    bm = binary_metrics(ext_bin_df.binary.values, binary_scores(p2, "restricted"))
                    rob_rows.append({"dataset": EXT_NAME, "model": info["display"], "key": key,
                                     "seed": seed, "corruption": cname,
                                     "accuracy": bm["accuracy"],
                                     "balanced_accuracy": bm["balanced_accuracy"],
                                     "macro_f1": bm["macro_f1"]})
            print(f"  {rid:<28} {len(CORRUPTIONS)} conditions evaluated"
                  f"{' (x2 datasets)' if ROBUST_ON_EXT else ''}")
            del model; gc.collect(); torch.cuda.empty_cache()

del ham_base, ham_sets
if ROBUST_ON_EXT:
    del ext_base, ext_sets
gc.collect()

rob_df = pd.DataFrame(rob_rows)
save_table(rob_df, "table6b_robustness_raw", "Raw per-seed robustness measurements")

def robustness_table(dataset: str) -> pd.DataFrame:
    d = rob_df[rob_df.dataset == dataset]
    if not len(d):
        return pd.DataFrame()
    piv = d.groupby(["model", "corruption"])["macro_f1"].mean().unstack()
    piv = piv[[c for c, _ in CORRUPTIONS if c in piv.columns]]
    out = piv.copy()
    clean = piv["clean"]
    corrupted_cols = [c for c in piv.columns if c != "clean"]
    out["mean_corrupted"] = piv[corrupted_cols].mean(axis=1)
    out["degradation_pct"] = 100 * (clean - out["mean_corrupted"]) / clean
    out["worst_case"] = piv[corrupted_cols].min(axis=1)
    out["worst_corruption"] = piv[corrupted_cols].idxmin(axis=1)
    return out.reset_index()

tab6 = robustness_table("HAM10000-test")
if len(tab6):
    print("=" * 175)
    print("TABLE 6 - Robustness under corruption (macro-F1, mean over "
          f"{len(CFG.robustness_seeds)} seeds, HAM10000 test, no retraining)")
    print("=" * 175)
    print(tab6.to_string(index=False, float_format=lambda v: f"{v:.4f}"))
    print("=" * 175)
    save_table(tab6, "table6_robustness_ham10000", "Table 6 - Corruption robustness (HAM10000)")
if ROBUST_ON_EXT:
    tab6b = robustness_table(EXT_NAME)
    if len(tab6b):
        print(f"\nTABLE 6b - Robustness under corruption ({EXT_NAME}, binary macro-F1)")
        print(tab6b.to_string(index=False, float_format=lambda v: f"{v:.4f}"))
        save_table(tab6b, "table6b_robustness_external",
           f"Table 6b - Corruption robustness ({EXT_NAME})")


Materialising corrupted copies once (shared by every model and seed)...


decoding eval cache:   0%|          | 0/1508 [00:00<?, ?it/s]

decoding eval cache:   0%|          | 0/2179 [00:00<?, ?it/s]

  11 conditions cached in 0h 00m 50s (5.69 GiB RAM); decoding is now done for the whole section.
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed42         11 conditions evaluated (x2 datasets)
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed123        11 conditions evaluated (x2 datasets)
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
  dinov3_vits16_seed2024       11 conditions evaluated (x2 datasets)
  convnextv2_tiny_seed42       11 conditions evaluated (x2 datasets)
  convnextv2_tiny_seed123      11 conditions evaluated (x2 datasets)
  convnextv2_tiny_seed2024     11 conditions evaluated (x2 datasets)
    [dinov3] token layout verified: 1 prefix (1 CLS + 0 register) + 196 patch tokens, width 384 -> feature dim 768
  deit3_small_seed42         

In [ ]:
# ============================================================================
# Cell 13.3 - Figure 4: degradation under corruption
# ============================================================================
if len(rob_df):
    d = rob_df[rob_df.dataset == "HAM10000-test"]
    piv = d.groupby(["model", "corruption"])["macro_f1"].mean().unstack()
    piv = piv[[c for c, _ in CORRUPTIONS if c in piv.columns]]
    rel = piv.div(piv["clean"], axis=0) * 100

    fig, axes = plt.subplots(1, 3, figsize=(19, 5.4))
    ax = axes[0]
    for model in piv.index:
        ax.plot(range(len(piv.columns)), piv.loc[model], "-o", ms=4, label=model)
    ax.set_xticks(range(len(piv.columns)))
    ax.set_xticklabels(piv.columns, rotation=45, ha="right", fontsize=7)
    ax.set_ylabel("macro F1"); ax.set_title("Absolute performance per corruption")
    ax.legend(fontsize=7); ax.grid(alpha=0.3)

    ax = axes[1]
    im = ax.imshow(rel.values, cmap="RdYlGn", vmin=60, vmax=105, aspect="auto")
    ax.set_xticks(range(len(rel.columns)))
    ax.set_xticklabels(rel.columns, rotation=45, ha="right", fontsize=7)
    ax.set_yticks(range(len(rel.index))); ax.set_yticklabels(rel.index, fontsize=8)
    for i in range(rel.shape[0]):
        for j in range(rel.shape[1]):
            ax.text(j, i, f"{rel.values[i, j]:.0f}", ha="center", va="center", fontsize=7)
    ax.set_title("Retained performance (% of clean macro-F1)")
    plt.colorbar(im, ax=ax, fraction=0.03)

    ax = axes[2]
    deg = tab6.set_index("model")["degradation_pct"]
    ax.barh(range(len(deg)), deg.values, color="#c1666b", edgecolor="black", linewidth=0.5)
    ax.set_yticks(range(len(deg))); ax.set_yticklabels(deg.index, fontsize=8)
    ax.set_xlabel("mean degradation (%)"); ax.set_title("Mean degradation over all corruptions")
    ax.grid(axis="x", alpha=0.3)
    plt.suptitle("Figure 4 - Corruption robustness", fontsize=13, y=1.03)
    plt.tight_layout()
    plt.savefig(CFG.fig_dir / "figure4_corruption_robustness.png", dpi=300, bbox_inches="tight")
    plt.show()

---
## 14. Computational Efficiency

**Experiment D.** Every quantity below is **measured on this runtime**, never taken from a paper.

* **Parameters / trainable parameters** — counted from the instantiated module (backbone + head).
* **FLOPs** — `fvcore.nn.FlopCountAnalysis` at batch 1. fvcore counts **multiply-accumulate
  operations**, so the column is labelled GMACs; the conventional "GFLOPs" figure is approximately
  2x this value. Operators that fvcore cannot trace (notably the selective-scan and WKV kernels)
  make the count unreliable, in which case the cell reports **`N/A (untraced ops: ...)`** rather
  than a number that would silently under-count.
* **Model size** — serialised `state_dict` size in MiB (fp32).
* **Peak GPU memory** — `torch.cuda.max_memory_allocated()` during a training-shaped
  forward+backward at the batch size actually used.
* **Latency / throughput** — median over 50 timed iterations after 10 warm-up iterations, with
  `torch.cuda.synchronize()` around every measurement; batch 1 for latency, batch 32 for throughput.
* **Training time** — the real per-epoch and total times recorded during Section 9.

In [ ]:
# ============================================================================
# Cell 14.1 - Table 7: measured computational efficiency
# ============================================================================
def measure_flops(model, img_size):
    try:
        from fvcore.nn import FlopCountAnalysis
        model_cpu = model.eval()
        fca = FlopCountAnalysis(model_cpu, torch.zeros(1, 3, img_size, img_size,
                                                       device=next(model.parameters()).device))
        fca.unsupported_ops_warnings(False); fca.uncalled_modules_warnings(False)
        total = fca.total()
        un = {k: v for k, v in fca.unsupported_ops().items() if v > 0}
        if total <= 0:
            return np.nan, "N/A (tracer returned 0)"
        if un:
            return total / 1e9, "partial: untraced " + ",".join(list(un)[:3])
        return total / 1e9, "complete"
    except Exception as e:  # noqa: BLE001
        return np.nan, f"N/A ({type(e).__name__})"

@torch.no_grad()
def measure_latency(model, img_size, batch, warmup=10, iters=50):
    model.eval()
    x = torch.randn(batch, 3, img_size, img_size, device=DEVICE)
    for _ in range(warmup):
        with torch.autocast("cuda", dtype=AMP_DTYPE, enabled=CFG.amp):
            model(x)
    torch.cuda.synchronize()
    ts = []
    for _ in range(iters):
        torch.cuda.synchronize(); t0 = time.perf_counter()
        with torch.autocast("cuda", dtype=AMP_DTYPE, enabled=CFG.amp):
            model(x)
        torch.cuda.synchronize()
        ts.append(time.perf_counter() - t0)
    return float(np.median(ts))

eff_rows = []
with Timer("efficiency_profiling", TIMINGS, verbose=False):
    for key in AVAILABLE_MODELS:
        info = MODEL_INFO[key]
        backbone, *_ = MODEL_BUILDERS[key](CFG.img_size)
        model = LesionClassifier(backbone, info["feat_dim"], NUM_CLASSES).to(DEVICE)
        n_total = sum(p.numel() for p in model.parameters())
        n_head = sum(p.numel() for p in model.head.parameters())
        size_mb = sum(p.numel() * p.element_size() for p in model.state_dict().values()) / 1024**2

        gmacs, flops_note = measure_flops(model, CFG.img_size)

        torch.cuda.empty_cache(); torch.cuda.reset_peak_memory_stats()
        model.train(); model.set_backbone_trainable(True)
        opt = torch.optim.AdamW(model.parameters(), lr=1e-5)
        x = torch.randn(BATCH_SIZE, 3, CFG.img_size, CFG.img_size, device=DEVICE)
        y = torch.randint(0, NUM_CLASSES, (BATCH_SIZE,), device=DEVICE)
        with torch.autocast("cuda", dtype=AMP_DTYPE, enabled=CFG.amp):
            loss = F.cross_entropy(model(x), y)
        loss.backward(); opt.step(); opt.zero_grad(set_to_none=True)
        peak_mem = torch.cuda.max_memory_allocated() / 1024**3
        del opt, x, y, loss
        gc.collect(); torch.cuda.empty_cache()

        lat1 = measure_latency(model, CFG.img_size, 1)
        lat32 = measure_latency(model, CFG.img_size, 32, warmup=5, iters=20)

        runs = [RESULTS[f"{key}_seed{s}"] for s in CFG.seeds if f"{key}_seed{s}" in RESULTS]
        eff_rows.append({
            "model": info["display"], "family": info["family"],
            "params_M": n_total / 1e6,
            "trainable_stage2_M": n_total / 1e6,
            "trainable_stage1_M": n_head / 1e6,
            "gmacs_at_224": gmacs, "flops_note": flops_note,
            "model_size_MiB": size_mb,
            "peak_train_mem_GiB": peak_mem,
            "latency_bs1_ms": lat1 * 1e3,
            "throughput_bs32_img_s": 32 / lat32,
            "train_s_per_epoch": float(np.mean([r["mean_epoch_s"] for r in runs])) if runs else np.nan,
            "train_total_s_per_seed": float(np.mean([r["run_time_s"] for r in runs])) if runs else np.nan,
            "train_total_h_all_seeds": (float(np.sum([r["run_time_s"] for r in runs])) / 3600
                                        if runs else np.nan),
        })
        print(f"  {info['display']:<26} {n_total/1e6:6.2f} M | "
              f"{(f'{gmacs:6.2f} GMACs' if np.isfinite(gmacs) else '   N/A     ')} | "
              f"{lat1*1e3:6.2f} ms/img | {32/lat32:7.1f} img/s | peak {peak_mem:.2f} GiB")
        del model, backbone
        gc.collect(); torch.cuda.empty_cache()

eff_df = pd.DataFrame(eff_rows)
if EXCLUDED_MODELS:
    excl = pd.DataFrame([{"model": f"{k} (EXCLUDED)", "family": MODEL_FAMILY[k]}
                         for k in EXCLUDED_MODELS])
    eff_df = pd.concat([eff_df, excl], ignore_index=True)
tab7 = eff_df[["model", "params_M", "gmacs_at_224", "flops_note", "model_size_MiB",
               "peak_train_mem_GiB", "latency_bs1_ms", "throughput_bs32_img_s",
               "train_s_per_epoch", "train_total_h_all_seeds"]]
print("=" * 165)
print("TABLE 7 - Measured computational efficiency (all values measured on this runtime)")
print(f"          GPU: {GPU_NAME} | batch size {BATCH_SIZE} | {AMP_DTYPE} autocast")
print("=" * 165)
print(tab7.to_string(index=False, float_format=lambda v: f"{v:10.3f}"))
print("=" * 165)
print("GMACs = fvcore multiply-accumulate count at batch 1 (GFLOPs ~ 2 x GMACs).")
print("N/A entries indicate operators fvcore cannot trace; no value is estimated in their place.")
save_table(tab7, "table7_computational_efficiency", "Table 7 - Measured computational efficiency")
save_table(eff_df, "table7_computational_efficiency_full")

In [ ]:
# ============================================================================
# Cell 14.2 - Figure 5: accuracy vs computational cost
# ============================================================================
if len(eff_df.dropna(subset=["latency_bs1_ms"])):
    e = eff_df.dropna(subset=["latency_bs1_ms"]).merge(
        tab3_full[["model", "macro_f1", "macro_f1_sd", "balanced_accuracy"]], on="model", how="left")
    fig, axes = plt.subplots(1, 3, figsize=(18, 5.2))
    palette = plt.cm.tab10(np.linspace(0, 1, max(len(e), 3)))

    for ax, xcol, xlabel in [
        (axes[0], "params_M", "parameters (M)"),
        (axes[1], "latency_bs1_ms", "inference latency, batch 1 (ms/image)"),
        (axes[2], "train_total_h_all_seeds", "total training time, all seeds (GPU-hours)"),
    ]:
        for i, r in e.iterrows():
            if not np.isfinite(r[xcol]):
                continue
            ax.errorbar(r[xcol], r["macro_f1"], yerr=np.nan_to_num(r["macro_f1_sd"]),
                        fmt="o", ms=11, capsize=4, color=palette[i % len(palette)],
                        label=r["model"])
            ax.annotate(r["model"], (r[xcol], r["macro_f1"]), textcoords="offset points",
                        xytext=(8, 6), fontsize=7)
        ax.set_xlabel(xlabel); ax.set_ylabel("HAM10000 test macro-F1")
        ax.grid(alpha=0.3)
    axes[0].set_title("Accuracy vs model size")
    axes[1].set_title("Accuracy vs latency")
    axes[2].set_title("Accuracy vs training cost")
    plt.suptitle("Figure 5 - Accuracy / cost trade-off (macro-F1 with SD over seeds)",
                 fontsize=13, y=1.03)
    plt.tight_layout()
    plt.savefig(CFG.fig_dir / "figure5_accuracy_vs_cost.png", dpi=300, bbox_inches="tight")
    plt.show()

---
## 15. Results Summary

The summary below is generated **from the measured results only**. Its language is constrained by
the statistical evidence: a model is called *best* only when its advantage is significant under
Holm-corrected McNemar tests in **all five seeds**; otherwise the wording is "highest-scoring,
but not significantly better", which is what the evidence actually supports.

In [ ]:
# ============================================================================
# Cell 15.1 - Automatic research summary
# ============================================================================
def best_by(df, col, label_col="model"):
    d = df.dropna(subset=[col])
    if not len(d):
        return None, np.nan
    r = d.loc[d[col].idxmax()]
    return r[label_col], float(r[col])

def worst_by(df, col, label_col="model"):
    d = df.dropna(subset=[col])
    if not len(d):
        return None, np.nan
    r = d.loc[d[col].idxmin()]
    return r[label_col], float(r[col])

lines = []
A = lines.append
A("=" * 96)
A("AUTOMATED RESEARCH SUMMARY")
A("=" * 96)
A(f"Generated : {time.strftime('%Y-%m-%d %H:%M:%S')}")
A(f"Hardware  : {GPU_NAME}")
A(f"Protocol  : lesion-disjoint 70/15/15 split (fingerprint {SPLIT_HASH}), "
  f"{len(CFG.seeds)} seeds {list(CFG.seeds)}, {CFG.total_epochs} epochs max, batch {BATCH_SIZE}")
A(f"Models    : {len(AVAILABLE_MODELS)} evaluated"
  + (f"; {len(EXCLUDED_MODELS)} EXCLUDED ({', '.join(EXCLUDED_MODELS)}) - see Compatibility Check"
     if EXCLUDED_MODELS else ""))
fb = [MODEL_INFO[k]["display"] for k in AVAILABLE_MODELS if MODEL_INFO[k]["is_fallback"]]
if fb:
    A(f"WARNING   : documented fallback architecture(s) used instead of the requested model: {fb}")
A("")

# --- 1. best on HAM10000 -----------------------------------------------------
tab3_eval = tab3_full[tab3_full.seeds > 0]
b_f1, v_f1 = best_by(tab3_eval, "macro_f1")
b_ba, v_ba = best_by(tab3_eval, "balanced_accuracy")
A("1. BEST MODEL ON HAM10000 (internal test)")
A(f"   Highest macro-F1          : {b_f1} ({v_f1:.4f})")
A(f"   Highest balanced accuracy : {b_ba} ({v_ba:.4f})")
if len(cons_df):
    winner_pairs = cons_df[cons_df.verdict.str.startswith("consistently")]
    beaten = [p for p in winner_pairs["pair"] if b_f1 in p]
    if len(beaten) == len(AVAILABLE_MODELS) - 1 and len(AVAILABLE_MODELS) > 1:
        A(f"   -> {b_f1} is significantly better than every other model in all "
          f"{len(CFG.seeds)} seeds (Holm-corrected McNemar).")
    elif beaten:
        A(f"   -> {b_f1} is significantly better than SOME models "
          f"({len(beaten)}/{len(AVAILABLE_MODELS) - 1} pairwise comparisons); "
          f"the remaining differences are not statistically supported.")
    else:
        A(f"   -> NO pairwise difference reached Holm-corrected significance in all seeds. "
          f"{b_f1} is the highest-scoring model but is NOT demonstrably better than the others.")
A("")

# --- 2. best on the external set ----------------------------------------------------------
A(f"2. BEST MODEL ON {EXT_NAME} (external validation, no retraining)")
if EXT_AVAILABLE:
    t4 = tab4_full.dropna(subset=["ext_balanced_accuracy"])
    b_ext, v_ext = best_by(t4, "ext_balanced_accuracy")
    A(f"   Highest external balanced acc : {b_ext} ({v_ext:.4f})")
    A(f"   External sample size          : {len(ext_df)} images "
      f"({int((ext_df.ext_label == 'mel').sum())} melanoma) - confidence intervals are wide.")
else:
    b_ext = None
    A(f"   NOT EVALUATED - {EXT_NAME} was unavailable. No external claim can be made.")
A("")

# --- 3. ranking stability ----------------------------------------------------
A("3. DOES THE RANKING CHANGE UNDER CROSS-DATASET EVALUATION?")
if EXT_AVAILABLE and len(tab4_full.dropna(subset=["ext_balanced_accuracy"])) > 1:
    r_int = tab3_eval.sort_values("macro_f1", ascending=False)["model"].tolist()
    r_ext = (tab4_full.dropna(subset=["ext_balanced_accuracy"])
             .sort_values("ext_balanced_accuracy", ascending=False)["model"].tolist())
    A(f"   HAM10000 ranking : {' > '.join(r_int)}")
    A(f"   External ranking : {' > '.join(r_ext)}")
    if r_int[:len(r_ext)] == r_ext:
        A("   -> The ranking is PRESERVED under domain shift.")
    else:
        A("   -> The ranking CHANGES under domain shift: internal HAM10000 performance is not a")
        A("      reliable predictor of external performance. This is a central finding.")
    dg = tab4_full.dropna(subset=["degradation_balanced_accuracy_pct"])
    if len(dg):
        least, lv = worst_by(dg, "degradation_balanced_accuracy_pct")
        A(f"   Smallest degradation: {least} ({lv:+.2f} % balanced accuracy)")
else:
    A(f"   NOT ASSESSABLE - {EXT_NAME} unavailable.")
A("")

# --- 4. robustness -----------------------------------------------------------
A("4. MOST ROBUST MODEL (corruption, no retraining)")
if len(tab6):
    b_rob, v_rob = worst_by(tab6, "degradation_pct")
    A(f"   Smallest mean macro-F1 degradation : {b_rob} ({v_rob:.2f} %)")
    wc, wv = best_by(tab6, "worst_case")
    A(f"   Best worst-case macro-F1           : {wc} ({wv:.4f})")
    A("   NOTE: no significance test is applied to the robustness ranking; these are descriptive")
    A("         means over seeds and corruption types.")
else:
    b_rob = None
    A("   NOT EVALUATED.")
A("")

# --- 5. efficiency -----------------------------------------------------------
A("5. MOST COMPUTATIONALLY EFFICIENT MODEL (measured)")
e_ok = eff_df.dropna(subset=["latency_bs1_ms"])
if len(e_ok):
    fast, fv = worst_by(e_ok, "latency_bs1_ms")
    small, sv = worst_by(e_ok, "params_M")
    thr, tv = best_by(e_ok, "throughput_bs32_img_s")
    cheap, cv = worst_by(e_ok, "train_total_h_all_seeds")
    A(f"   Lowest latency      : {fast} ({fv:.2f} ms/image, batch 1)")
    A(f"   Highest throughput  : {thr} ({tv:.1f} images/s, batch 32)")
    A(f"   Fewest parameters   : {small} ({sv:.2f} M)")
    A(f"   Cheapest to train   : {cheap} ({cv:.2f} GPU-hours for all seeds)")
    merged = e_ok.merge(tab3_full[["model", "macro_f1"]], on="model", how="left").dropna(subset=["macro_f1"])
    if len(merged):
        merged["f1_per_ms"] = merged["macro_f1"] / merged["latency_bs1_ms"]
        eff_best, _ = best_by(merged, "f1_per_ms")
        A(f"   Best accuracy/latency ratio : {eff_best}")
A("")

# --- 6. seed stability -------------------------------------------------------
A("6. IS PERFORMANCE STABLE ACROSS SEEDS?")
for _, r in tab3_eval.iterrows():
    sd, mean = r["macro_f1_sd"], r["macro_f1"]
    cv = 100 * sd / mean if (np.isfinite(sd) and mean) else np.nan
    verdict = ("stable" if cv < 2 else "moderately variable" if cv < 5 else "UNSTABLE")
    A(f"   {r['model']:<28} macro-F1 {mean:.4f} +/- {sd:.4f}  (CV {cv:.2f} % -> {verdict})")
A("   A coefficient of variation above ~5 % means seed-to-seed noise is comparable to the")
A("   between-model differences, and single-seed comparisons would be unreliable.")
A("")

# --- 7. guarded conclusion ---------------------------------------------------
A("7. WHAT THIS STUDY DOES AND DOES NOT SHOW")
A("   - Under an identical recipe and a lesion-disjoint split, the highest-scoring architecture")
A(f"     on HAM10000 is {b_f1}.")
if len(cons_df) and not len(cons_df[cons_df.verdict.str.startswith('consistently')]):
    A("   - NO pairwise difference survived Holm correction in all seeds. The four architectures")
    A("     should be regarded as statistically indistinguishable on this benchmark.")
A("   - These are computer-vision benchmark results. They say nothing about clinical readiness,")
A("     diagnostic safety, or deployment suitability. See Section 17.")
A("=" * 96)

SUMMARY = "\n".join(lines)
print(SUMMARY)
(CFG.out_dir / "research_summary.txt").write_text(SUMMARY)

---
## 16. Reproducibility Information

Everything needed to reproduce or audit this run — package versions, GPU, seeds, split
fingerprint, class weights, per-run configuration, per-seed metrics, and the **measured** compute
budget — is printed here and exported to `results/`.

In [ ]:
# ============================================================================
# Cell 16.1 - Environment, seeds, and measured compute budget
# ============================================================================
import importlib.metadata as md

def ver(p):
    try:
        return md.version(p)
    except Exception:  # noqa: BLE001
        return "not installed"

env = OrderedDict([
    ("timestamp", time.strftime("%Y-%m-%d %H:%M:%S %Z")),
    ("python", sys.version.split()[0]),
    ("platform", platform.platform()),
    ("gpu", GPU_NAME),
    ("cuda_torch", torch.version.cuda),
    ("cudnn", torch.backends.cudnn.version()),
    ("torch", torch.__version__),
    ("torchvision", ver("torchvision")),
    ("timm", ver("timm")),
    ("transformers", ver("transformers")),
    ("mamba_ssm", ver("mamba-ssm")),
    ("causal_conv1d", ver("causal-conv1d")),
    ("numpy", np.__version__), ("pandas", pd.__version__),
    ("scikit-learn", ver("scikit-learn")), ("statsmodels", ver("statsmodels")),
    ("fvcore", ver("fvcore")),
    ("deterministic_mode", DETERMINISTIC),
    ("amp_dtype", str(AMP_DTYPE)),
    ("seeds", list(CFG.seeds)),
    ("split_seed", CFG.split_seed),
    ("split_fingerprint", SPLIT_HASH),
    ("grouping_key", GROUP_KEY),
    ("label_mapping_hash", MAPPING_HASH),
    ("batch_size", BATCH_SIZE),
    ("steps_per_epoch", STEPS_PER_EPOCH),
    ("n_train", len(train_df)), ("n_val", len(val_df)), ("n_test", len(test_df)),
    ("n_external", len(ext_df) if EXT_AVAILABLE else 0),
    ("models_evaluated", [MODEL_INFO[k]["display"] for k in AVAILABLE_MODELS]),
    ("models_excluded", EXCLUDED_MODELS),
    ("test_set_access_log", GUARD.report()),
])
print("=" * 90)
print("REPRODUCIBILITY RECORD")
print("=" * 90)
for k, v in env.items():
    print(f"  {k:24s}: {v}")

# ------------------------------------------------------- compute budget ------
train_s = TIMINGS.get("training_total", 0.0)
ext_eval_s = TIMINGS.get("evaluation_external", 0.0)
rob_s = TIMINGS.get("robustness_evaluation", 0.0)
stat_s = TIMINGS.get("statistical_testing", 0.0)
eff_s = TIMINGS.get("efficiency_profiling", 0.0)
test_s = TIMINGS.get("evaluation_ham_test", 0.0)
data_s = (TIMINGS.get("dataset_acquisition_ham", 0.0) + TIMINGS.get("dataset_acquisition_external", 0.0)
          + TIMINGS.get("dataset_resize_cache", 0.0) + TIMINGS.get("leakage_audit_phase1", 0.0)
          + TIMINGS.get("batch_size_search", 0.0))
gpu_s = train_s + ext_eval_s + rob_s + eff_s + test_s + TIMINGS.get("batch_size_search", 0.0)
wall_s = time.perf_counter() - NOTEBOOK_T0
n_runs = max(len(RESULTS), 1)

budget = pd.DataFrame([
    ("Dataset preparation + audit", data_s / 60, "minutes"),
    ("Main training", train_s / 3600, "GPU-hours"),
    ("HAM10000 test inference", test_s / 60, "minutes"),
    (f"External validation ({EXT_NAME})", ext_eval_s / 60, "minutes"),
    ("Corruption robustness", rob_s / 3600, "GPU-hours"),
    ("Efficiency profiling", eff_s / 60, "minutes"),
    ("Statistical testing", stat_s / 60, "minutes"),
    ("TOTAL GPU experiment time", gpu_s / 3600, "GPU-hours"),
    ("TOTAL wall-clock time", wall_s / 3600, "hours"),
], columns=["phase", "value", "unit"])

print("\n" + "=" * 90)
print("MEASURED COMPUTE BUDGET  (computed from time.perf_counter(), not estimated)")
print("=" * 90)
print(budget.to_string(index=False, float_format=lambda v: f"{v:9.3f}"))
print("-" * 90)
print(f"  Runs completed          : {n_runs}")
print(f"  Epochs measured         : {len(tracker.epoch_times)}")
print(f"  Average time / epoch    : {tracker.mean_epoch:.1f} s")
print(f"  Average time / run      : {fmt_hms(train_s / n_runs)}")
print(f"  Average time / model    : {fmt_hms(train_s / max(len(AVAILABLE_MODELS), 1))}")
print(f"  Average time / seed     : {fmt_hms(train_s / max(len(CFG.seeds), 1))}")
tgt_lo, tgt_hi = 12, 20
gpu_h = gpu_s / 3600
print(f"\n  Target budget           : {tgt_lo}-{tgt_hi} GPU-hours on an L4")
print(f"  Actual                  : {gpu_h:.2f} GPU-hours -> "
      f"{'WITHIN budget' if tgt_lo <= gpu_h <= tgt_hi else 'BELOW budget' if gpu_h < tgt_lo else 'ABOVE budget'}")
if gpu_h < tgt_lo:
    print("  (Below budget is expected when fewer than four architectures were available, when")
    print("   early stopping triggered, or when a cached resize speeds up dataloading.)")
print("=" * 90)

save_table(budget, "table8_compute_budget", "Measured compute budget")
json.dump({"environment": {k: str(v) for k, v in env.items()},
           "timings_seconds": TIMINGS,
           "epoch_times_seconds": tracker.epoch_times,
           "run_times_seconds": tracker.run_times,
           "config": {k: (list(v) if isinstance(v, tuple) else str(v))
                      for k, v in asdict(CFG).items()}},
          open(CFG.out_dir / "reproducibility.json", "w"), indent=2, default=str)
print(f"\nExported: {CFG.out_dir / 'reproducibility.json'}")

# ---- experiment manifest: one auditable row per run -------------------------
manifest_rows = []
for rid, r in RESULTS.items():
    key, seed = r["key"], r["seed"]
    info = MODEL_INFO[key]
    hist = pd.DataFrame(r["history"])
    manifest_rows.append({
        "run_id": rid,
        "model": info["display"],
        "family": info["family"],
        "checkpoint_source": info["source"],
        "is_documented_fallback": info.get("is_fallback", False),
        "seed": seed,
        "dataset": "HAM10000",
        "split_seed": CFG.split_seed,
        "split_hash": SPLIT_HASH,
        "grouping_key": GROUP_KEY,
        "n_train": len(train_df), "n_val": len(val_df), "n_test": len(test_df),
        "img_size": CFG.img_size,
        "batch_size": BATCH_SIZE,
        "steps_per_epoch": STEPS_PER_EPOCH,
        "optimizer": "AdamW(betas=0.9/0.999)",
        "scheduler": "cosine + 10% linear warm-up (stage 2)",
        "weight_decay": CFG.weight_decay,
        "lr_head_stage1": CFG.lr_head_stage1,
        "lr_head_stage2": CFG.lr_head_stage2,
        "lr_backbone": BACKBONE_LR.get(key, np.nan),
        "lr_selected_on": "validation macro-F1" if CFG.lr_search else "fixed default",
        "epochs_planned": CFG.total_epochs,
        "epochs_frozen": CFG.stage1_epochs,
        "epochs_done": r["epochs_done"],
        "early_stopped": r["epochs_done"] < CFG.total_epochs,
        "best_epoch": r["best"]["epoch"],
        "best_stage": r["best"].get("stage", np.nan),
        "selected_ckpt_is_linear_probe": r["best"].get("stage", 2) == 1,
        "best_val_macro_f1": r["best"]["macro_f1"],
        "drop_path": info.get("drop_path", np.nan),
        "norm_mean": str(info.get("norm_mean", "")),
        "norm_std": str(info.get("norm_std", "")),
        "amp": CFG.amp, "amp_dtype": str(AMP_DTYPE),
        "deterministic": DETERMINISTIC,
        "train_time_s": r["run_time_s"],
        "mean_epoch_s": r["mean_epoch_s"],
        "throughput_bound": CALIB.get(key, {}).get("bound", "not measured"),
        "gpu": GPU_NAME,
        "torch": torch.__version__,
        "timestamp_utc": datetime.now(timezone.utc).isoformat(timespec="seconds"),
    })
manifest = pd.DataFrame(manifest_rows)
save_table(manifest, "experiment_manifest", "Experiment manifest (one row per run)")
print("\n" + "=" * 84)
print(f"EXPERIMENT MANIFEST - {len(manifest)} runs, {len(manifest.columns)} recorded fields")
print("=" * 84)
print(manifest[["run_id", "seed", "lr_backbone", "epochs_done", "early_stopped",
                "best_val_macro_f1", "train_time_s", "throughput_bound"]]
      .to_string(index=False, float_format=lambda v: f"{v:.5g}"))
print(f"\nFull manifest -> {CFG.tab_dir}/experiment_manifest.csv")
# A run whose best epoch is its last epoch had not converged: the epoch budget, not the
# model, decided where it stopped. Reporting such a run as the architecture's
# performance overstates what was measured.
_late = manifest[(~manifest.early_stopped) & (manifest.best_epoch >= manifest.epochs_done)]
if len(_late):
    print(f"\n  WARNING - {len(_late)}/{len(manifest)} runs peaked at their FINAL epoch with no")
    print("  early stop, so they were still improving when the budget ended. These results")
    print("  describe under-trained models. Raise CFG.stage2_epochs and re-run, or state")
    print("  explicitly that the comparison is at a fixed, non-converged budget.")
    print("  " + ", ".join(_late.run_id.tolist()))

_lp = manifest[manifest.selected_ckpt_is_linear_probe]
if len(_lp):
    print("\n  WARNING - for these runs the best VALIDATION score came from stage 1, so the")
    print("  selected checkpoint is a frozen linear probe, not a fine-tuned model. The")
    print("  selection is legitimate (validation-based), but it must be reported as such:")
    print("  " + ", ".join(_lp.run_id.tolist()))


---
## 17. Limitations

### 17.1 Dataset and label limitations

1. **HAM10000 is severely imbalanced** (≈67 % `nv`; `df` and `vasc` below 1.5 % each). Rare-class
   metrics rest on a few dozen test images, so their per-class F1 and sensitivity have very wide
   sampling error, and class-weighted loss mitigates but does not remove this.
2. **No patient identifier exists in the public HAM10000 metadata.** The split is lesion-disjoint,
   which removes the dominant leakage path (multiple captures of one lesion), but a single patient
   may still contribute lesions to more than one partition. A patient-disjoint split is not
   constructible from the released metadata; this is a limitation of the data, not of the protocol.
3. **Ground truth is heterogeneous.** HAM10000 labels come from histopathology, follow-up,
   expert consensus, or confocal microscopy (`dx_type`), and these differ in reliability.
4. **PH2 is small** — 200 images, only 40 melanomas. Even a perfect classifier would have a wide
   confidence interval on this sample; PH2 results are indicative, not conclusive.
5. **The two datasets have incompatible label spaces.** The seven HAM10000 classes were projected
   onto a binary melanoma-vs-nevus task using the mapping frozen in Section 3.5. Five HAM10000
   classes have no PH2 counterpart and are excluded from the cross-dataset comparison, so
   Experiment B evaluates a strictly easier task than Experiment A. Degradation is therefore
   computed against the internal *binary* reference, not against the 7-class result.
6. **PH2's atypical nevi are mapped to the nevus class.** They are dysplastic nevi rather than
   melanomas, but they are the hardest negatives in the set, and a different clinically motivated
   mapping (e.g. treating them as a third category, or excluding them) would change the reported
   specificity. The chosen mapping is stated in advance and is not tuned to improve results.

### 17.2 Domain shift

PH2 was acquired at a single centre with one dermoscope under controlled magnification, whereas
HAM10000 aggregates images from multiple sites, devices, and decades. Cross-dataset differences
therefore confound *architecture generalisation* with *acquisition characteristics*, and the
decision threshold was deliberately left at 0.5 rather than being recalibrated on PH2 (which would
convert an external test set into a validation set).

### 17.3 Methodological limitations

7. **Three seeds give very wide t-intervals.** The 95 % CI multiplier at `df = 4` is 2.776. The
   seed-level CIs should be read as a coarse stability indicator; the McNemar test on paired
   per-example predictions is the stronger evidence.
8. **No hyperparameter search was performed.** A single shared recipe is used for every model,
   which is the correct control for an architecture comparison but may disadvantage a model whose
   optimum lies elsewhere. The absolute numbers are therefore lower bounds on what each
   architecture can achieve.
9. **The compute budget caps training at 20 epochs.** Longer schedules could change the ranking,
   particularly for the architectures with the least mature pretraining recipes.
10. **Bit-exact reproducibility is not claimed** (`DETERMINISTIC = False` by default); run-to-run
    variation is measured and reported instead.
11. **FLOPs are partially untraceable.** The selective-scan and WKV kernels are opaque to fvcore;
    those entries are reported as `N/A` rather than being under-counted.
12. **The corruption suite is deliberately small** — five corruption types at two severities,
    synthetic and applied post-hoc. It is not a substitute for a full ImageNet-C-style protocol,
    and it does not model hair occlusion, ruler marks, gel bubbles, or vignetting.

### 17.4 Clinical limitations

13. **This study does not establish clinical readiness.** It measures computer-vision performance
    on curated retrospective benchmarks under a fixed compute budget. It involves no prospective
    data, no clinician comparison, no calibration analysis, no assessment across skin phototypes,
    no failure-mode analysis, and no regulatory evaluation. Nothing here should be read as
    evidence that any of these models is suitable for diagnostic use.
14. **Skin-tone coverage is unmeasured.** Neither HAM10000 nor PH2 records Fitzpatrick phototype,
    and both are dominated by lighter skin. Performance on darker skin is unknown and cannot be
    inferred from these results.

### 17.4 Limits of the evaluation-protocol ablation (Section 18)

11. **One seed.** The ablation is screening-budget. Its result is reported as a level effect unless
    the spread of inflation across architectures exceeds twice the seed-to-seed SD already measured
    in Table 3b, in which case it is promoted to the full seed count. The promotion rule is fixed in
    advance so the decision is not made after seeing which answer is more interesting.
12. **The two protocols have different test sets,** so their scores cannot be compared with a
    paired test. What is compared is what each protocol would *report* — which is exactly the
    quantity at issue — not two measurements of the same sample.
13. **The leaky protocol is a reconstruction, not a citation.** It reproduces the most common
    published practice (stratified random split at image level). Individual published pipelines
    differ in augmentation, resolution and backbone, so the measured inflation is what this
    protocol costs *in this setting*, and is not a correction factor to be subtracted from any
    particular published number.
14. **Duplicate handling still applies to both arms.** The pixel-identical merge of Section 5 is
    performed before either split, so the ablation isolates lesion-level leakage rather than
    exact-duplicate leakage, which is controlled in both arms.

### 17.5 Interpretive limitation

15. **Performance differences cannot be attributed to architecture.** See Section 1.1. Any ranking
    reported here is a ranking of pretrained configurations under one fixed transfer budget, and a
    different budget, a different pretraining corpus, or a per-model hyperparameter search beyond
    the backbone learning rate could change it.


---

## 18. Evaluation-protocol ablation: how much does an image-level split inflate results?

Everything above uses a lesion-disjoint split. Most published HAM10000 results do not — they
partition at image level, which places multiple photographs of the *same physical lesion* on both
sides of the split. This section measures what that costs, using the four architectures already
benchmarked.

**The scientific question:** is the inflation a fixed offset that leaves model *rankings* intact,
or does it vary by architecture — in which case protocol choice does not merely inflate numbers,
it can reorder conclusions?

**Design.** Exactly one thing changes: the split. The same `run_experiment` function, the same
backbone learning rates selected in Section 9.2c, the same augmentation, batch size, schedule,
epoch budget, seed and class-weighting *rule* are used for both protocols. Class weights and
steps-per-epoch are recomputed from each training split because they are properties of the split,
not constants. Using two separate training implementations would confound leakage with
implementation drift, so a single parameterised code path serves both.

**Screening budget.** One seed (Rule: 1 seed for exploratory work). This measures an effect that
the literature reports at 15–20 accuracy points; it does not need three seeds to be visible. If the
effect turns out to be smaller than the seed-to-seed SD already measured in Table 3b, it will be
reported as inconclusive rather than promoted.

**A decomposition that costs nothing extra.** The leaky test set splits into images whose lesion
also appears in the leaky training set (*contaminated*) and images whose lesion does not
(*clean*). Scoring those two subsets separately localises the inflation directly, from predictions
that have already been computed.

In [ ]:
# ============================================================================
# Cell 18.1 - Construct the leakage-prone split and quantify the contamination
# ============================================================================
from sklearn.model_selection import StratifiedShuffleSplit

RUN_LEAKAGE_ABLATION = True          # set False to skip Section 18 entirely
# Run 1's single-seed ablation showed a ranking reversal that run 2 did not reproduce -
# the disjoint ranking itself flipped between runs. A one-seed ablation cannot separate a
# protocol effect from seed noise, and the promotion rule fired once and not the other
# time. The ablation is therefore run at the full seed count.
# v3: the protocol ablation carries the paper's headline claim, so it runs at the
# SAME seed count as the main experiment. With several architectures the quantity
# under test is the BETWEEN-architecture spread in inflation, and at n=3 that spread
# cannot be separated from seed noise. Set to 3 to halve the ablation's cost.
LEAK_ABLATION_SEEDS = 5
LEAK_SEEDS = tuple(CFG.seeds[:LEAK_ABLATION_SEEDS])
LEAK_SEED = LEAK_SEEDS[0]            # kept for the single-seed comparison plots

# Image-level stratified split with the SAME ratios and the SAME split seed as Section 6.
# `group_id` is deliberately ignored - that is precisely the flaw being measured.
_sss1 = StratifiedShuffleSplit(n_splits=1, test_size=0.30, random_state=CFG.split_seed)
_tr_idx, _rest_idx = next(_sss1.split(ham, ham.label_idx.values))
_rest = ham.iloc[_rest_idx]
_sss2 = StratifiedShuffleSplit(n_splits=1, test_size=0.50, random_state=CFG.split_seed)
_va_rel, _te_rel = next(_sss2.split(_rest, _rest.label_idx.values))

leak_train = ham.iloc[_tr_idx].reset_index(drop=True)
leak_val   = _rest.iloc[_va_rel].reset_index(drop=True)
leak_test  = _rest.iloc[_te_rel].reset_index(drop=True)
LEAK_SPLIT_HASH = hashlib.sha256(
    "|".join(sorted([f"{r.image_id}:train" for r in leak_train.itertuples()] +
                    [f"{r.image_id}:val" for r in leak_val.itertuples()] +
                    [f"{r.image_id}:test" for r in leak_test.itertuples()]))
    .encode()).hexdigest()[:16]

# ---- contamination diagnostics (zero compute) -------------------------------
train_groups = set(leak_train.group_id)
val_groups = set(leak_val.group_id)
test_groups = set(leak_test.group_id)
leak_test = leak_test.assign(contaminated=leak_test.group_id.isin(train_groups))
leak_val = leak_val.assign(contaminated=leak_val.group_id.isin(train_groups))

n_groups_total = ham.group_id.nunique()
crossing = sum(1 for g in ham.group_id.unique()
               if len({"train" if g in train_groups else "",
                       "val" if g in val_groups else "",
                       "test" if g in test_groups else ""} - {""}) > 1)
n_contam = int(leak_test.contaminated.sum())

print("=" * 88)
print("LEAKAGE-PRONE PROTOCOL - contamination audit")
print("=" * 88)
print(f"  Split sizes            : train {len(leak_train)} / val {len(leak_val)} / "
      f"test {len(leak_test)}")
print(f"  Lesion-disjoint sizes  : train {len(train_df)} / val {len(val_df)} / test {len(test_df)}")
print(f"  Lesions spanning >1 partition : {crossing}/{n_groups_total} "
      f"({100 * crossing / n_groups_total:.2f} %)")
print(f"  Test images whose lesion is in TRAIN : {n_contam}/{len(leak_test)} "
      f"({100 * n_contam / len(leak_test):.2f} %)   <- the contaminated subset")
print(f"  Val images whose lesion is in TRAIN  : {int(leak_val.contaminated.sum())}/{len(leak_val)} "
      f"({100 * leak_val.contaminated.mean():.2f} %)")
print(f"  Leaky split fingerprint : {LEAK_SPLIT_HASH}")
print(f"  Lesion-disjoint fingerprint : {SPLIT_HASH}")

# sanity: the lesion-disjoint split must show zero contamination by the same measure
_dj_contam = int(test_df.group_id.isin(set(train_df.group_id)).sum())
record("lesion-disjoint test set has zero train-lesion overlap", _dj_contam == 0,
       f"{_dj_contam} test images share a lesion with train")
if _dj_contam != 0:
    raise RuntimeError(
        f"Control failed: {_dj_contam} lesion-disjoint test images share a lesion with train. "
        "The ablation compares against a contaminated reference, so its result would be "
        "meaningless - fix Section 6 before continuing.")
print(f"\n  Control - same measure on the lesion-disjoint split : {_dj_contam}/{len(test_df)} "
      f"(must be 0)")
print("=" * 88)

leak_stats = pd.DataFrame([{
    "protocol": "image-level random (leakage-prone)", "split_hash": LEAK_SPLIT_HASH,
    "n_train": len(leak_train), "n_val": len(leak_val), "n_test": len(leak_test),
    "lesions_spanning_partitions": crossing, "lesions_total": n_groups_total,
    "pct_lesions_spanning": 100 * crossing / n_groups_total,
    "test_contaminated": n_contam, "pct_test_contaminated": 100 * n_contam / len(leak_test)},
    {"protocol": "lesion-disjoint (this study)", "split_hash": SPLIT_HASH,
     "n_train": len(train_df), "n_val": len(val_df), "n_test": len(test_df),
     "lesions_spanning_partitions": 0, "lesions_total": n_groups_total,
     "pct_lesions_spanning": 0.0, "test_contaminated": _dj_contam,
     "pct_test_contaminated": 100 * _dj_contam / len(test_df)}])
save_table(leak_stats, "table9a_protocol_contamination",
           "Table 9a - Contamination under each evaluation protocol")

LEAK_PROTOCOL = make_protocol(leak_train, leak_val, leak_test, LEAK_SPLIT_HASH,
                              "image-level random (leakage-prone)", "_leaky")
print(f"\nClass weights, lesion-disjoint : {np.round(class_weights, 3).tolist()}")
print(f"Class weights, leaky protocol  : {np.round(LEAK_PROTOCOL['weights_np'], 3).tolist()}")
print("(Recomputed from each training split by the same rule - they are a property of the split.)")


In [ ]:
# ============================================================================
# Cell 18.2 - Train under the leakage-prone protocol (identical code path)
# ============================================================================
LEAK_RESULTS, LEAK_PRED = {}, {}

if RUN_LEAKAGE_ABLATION and AVAILABLE_MODELS:
    leak_tracker = RunTracker(len(AVAILABLE_MODELS) * len(LEAK_SEEDS), CFG.total_epochs)
    with Timer("leakage_ablation_training", TIMINGS, verbose=False):
        for key, LEAK_SEED in [(k, s) for k in AVAILABLE_MODELS for s in LEAK_SEEDS]:
            run_id = f"{key}_seed{LEAK_SEED}_leaky"
            ck = CFG.ckpt_dir / run_id
            if (ck / "best.pt").exists() and (ck / "config.json").exists():
                try:
                    prev = json.loads((ck / "config.json").read_text())
                    if (prev.get("split_hash") == LEAK_SPLIT_HASH
                            and abs(float(prev.get("lr_backbone", -1)) - BACKBONE_LR[key]) < 1e-12):
                        print(f"[skip] {run_id} already trained under this leaky split")
                        hist = pd.read_csv(ck / "history.csv")
                        LEAK_RESULTS[run_id] = {
                            "run_id": run_id, "key": key, "seed": LEAK_SEED,
                            "protocol": LEAK_PROTOCOL["name"], "split_hash": LEAK_SPLIT_HASH,
                            "best": {"macro_f1": float(hist.val_macro_f1.max()),
                                     "epoch": int(hist.val_macro_f1.idxmax()) + 1},
                            "epochs_done": len(hist), "run_time_s": float(hist.epoch_time_s.sum()),
                            "mean_epoch_s": float(hist.epoch_time_s.mean()),
                            "history": hist.to_dict("records"), "ckpt": str(ck / "best.pt")}
                        continue
                except Exception as e:  # noqa: BLE001
                    print(f"[retrain] {run_id}: {type(e).__name__}")
            try:
                LEAK_RESULTS[run_id] = run_experiment(key, LEAK_SEED, leak_tracker,
                                                      protocol=LEAK_PROTOCOL)
            except Exception as e:  # noqa: BLE001
                print(f"[FAILED] {run_id}: {type(e).__name__}: {e}")
                EXCLUDED_MODELS.setdefault(key, f"leakage ablation failed: {type(e).__name__}")
    print(f"\nLeakage-ablation training time: {fmt_hms(TIMINGS.get('leakage_ablation_training', 0))}")
else:
    print("Leakage ablation skipped (RUN_LEAKAGE_ABLATION = False or no models available).")

# ---- evaluate on the leaky test set, then decompose it ----------------------
leak_rows = []
for run_id, r in LEAK_RESULTS.items():
    key = r["key"]
    info = MODEL_INFO[key]
    _, eval_tf = build_transforms(info["mean"], info["std"], CFG.img_size)
    backbone, *_ = MODEL_BUILDERS[key](CFG.img_size)
    model = LesionClassifier(backbone, info["feat_dim"], NUM_CLASSES).to(DEVICE)
    state = torch.load(r["ckpt"], map_location=DEVICE, weights_only=False)
    model.load_state_dict(state["model"])
    loader = make_loader(leak_test, eval_tf, BATCH_SIZE * 2, False, LEAK_SEED)
    ev = evaluate(model, loader, return_probs=True)
    LEAK_PRED[run_id] = ev
    contam = leak_test.contaminated.values

    for subset, mask in [("all", np.ones(len(leak_test), bool)),
                         ("contaminated", contam), ("clean", ~contam)]:
        if mask.sum() < 10:
            continue
        m = compute_metrics(ev["y_true"][mask], ev["y_pred"][mask],
                            ev["probs"][mask], class_names=CLASSES)
        leak_rows.append({"model": info["display"], "key": key, "seed": LEAK_SEED,
                          "subset": subset, "n": int(mask.sum()),
                          "accuracy": m["accuracy"],
                          "balanced_accuracy": m["balanced_accuracy"],
                          "macro_f1": m["macro_f1"]})
    np.savez_compressed(CFG.pred_dir / f"{run_id}_leaky_test.npz",
                        y_true=ev["y_true"], y_pred=ev["y_pred"], probs=ev["probs"],
                        contaminated=contam)
    del model, backbone, loader
    gc.collect(); torch.cuda.empty_cache()

leak_eval = pd.DataFrame(leak_rows)
if len(leak_eval):
    print("\n" + "=" * 110)
    print(f"TABLE 9b - Performance under the leakage-prone protocol, decomposed "
          f"(seed {LEAK_SEED})")
    print("=" * 110)
    print(leak_eval.to_string(index=False, float_format=lambda v: f"{v:.4f}"))
    print("=" * 110)
    print("`contaminated` = test images whose lesion also appears in the training split.")
    save_table(leak_eval, "table9b_leaky_decomposition",
               "Table 9b - Leaky-protocol performance on contaminated vs clean test images")



EXPERIMENT
  Model        : DINOv3 ViT-S/16   [Self-supervised ViT (foundation model)]
  Weights      : timm:vit_small_patch16_dinov3.lvd1689m
  Seed         : 42
  GPU          : NVIDIA L4
  Image size   : 224
  Epochs       : 20 (4 frozen + 16 FT)
  Batch size   : 64
  LR           : head 0.001/0.0001 | backbone 0.0001
  Protocol     : image-level random (leakage-prone)
  Split        : 1ce9960e8363470f  (train 7010 / val 1502 / test 1503)

-- Stage 1: 4 epochs, 0.01 M trainable parameters


train:   0%|          | 0/110 [00:00<?, ?it/s]

    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
   ep  1/20 | train loss 1.3459 acc 0.5765 | val loss 1.1738 bAcc 0.5687 mF1 0.4107 | 22.4s  <- best (checkpoint saved)


train:   0%|          | 0/110 [00:00<?, ?it/s]

   ep  2/20 | train loss 0.9539 acc 0.6813 | val loss 1.0595 bAcc 0.6096 mF1 0.4960 | 21.7s  <- best (checkpoint saved)


...

   ep 16/20 | train loss 0.1119 acc 0.9240 | val loss 0.7001 bAcc 0.7774 mF1 0.7279 | 30.2s


train:   0%|          | 0/110 [00:00<?, ?it/s]

   ep 17/20 | train loss 0.0941 acc 0.9375 | val loss 0.7950 bAcc 0.7578 mF1 0.7305 | 30.2s


train:   0%|          | 0/110 [00:00<?, ?it/s]

   ep 18/20 | train loss 0.0884 acc 0.9449 | val loss 0.8354 bAcc 0.7649 mF1 0.7519 | 30.2s
   early stopping: no val macro-F1 improvement for 3 epochs
-- run finished in 0h 08m 30s | best val macro-F1 0.7664 @ epoch 15
-- estimated remaining training time: 0h 19m 38s (upper bound: 37 epochs x 31.8s mean; early stopping can only reduce this)

Leakage-ablation training time: 5h 53m 56s
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
    [dinov3] token layout verified: 5 prefix (1 CLS + 4 register) + 196 patch tokens, width 384 -> feature dim 768
    [dinov3] token layout verified: 1

In [ ]:
# ============================================================================
# Cell 18.3 - Table 9c and Figure 7: the inflation, per architecture
# ============================================================================
infl_rows = []
# Averaged over LEAK_SEEDS. A single-seed inflation estimate cannot be separated from
# seed noise: in the first complete run the disjoint ranking itself flipped between the
# two runs, so any conclusion drawn from one seed was a coin flip.
for key in AVAILABLE_MODELS:
    per_seed = []
    for sd in LEAK_SEEDS:
        rid_dj, rid_lk = f"{key}_seed{sd}", f"{key}_seed{sd}_leaky"
        if rid_dj not in TEST_PRED or rid_lk not in LEAK_PRED:
            continue
        dj = compute_metrics(TEST_PRED[rid_dj]["y_true"], TEST_PRED[rid_dj]["y_pred"],
                             TEST_PRED[rid_dj]["probs"], class_names=CLASSES)
        lk = compute_metrics(LEAK_PRED[rid_lk]["y_true"], LEAK_PRED[rid_lk]["y_pred"],
                             LEAK_PRED[rid_lk]["probs"], class_names=CLASSES)
        per_seed.append({m: (dj[m], lk[m]) for m in
                         ("accuracy", "balanced_accuracy", "macro_f1")} | {"seed": sd})
    if not per_seed:
        continue
    row = {"model": MODEL_INFO[key]["display"], "key": key, "n_seeds": len(per_seed)}
    for met in ("accuracy", "balanced_accuracy", "macro_f1"):
        d = np.array([p[met][0] for p in per_seed])
        l = np.array([p[met][1] for p in per_seed])
        row[f"{met}_disjoint"] = float(d.mean())
        row[f"{met}_leaky"] = float(l.mean())
        row[f"{met}_inflation"] = float((l - d).mean())
        row[f"{met}_inflation_sd"] = float((l - d).std(ddof=1)) if len(d) > 1 else np.nan
    clean = leak_eval[(leak_eval.key == key) & (leak_eval.subset == "clean")]
    cont = leak_eval[(leak_eval.key == key) & (leak_eval.subset == "contaminated")]
    row["macro_f1_leaky_clean"] = float(clean.macro_f1.mean()) if len(clean) else np.nan
    row["macro_f1_leaky_contaminated"] = float(cont.macro_f1.mean()) if len(cont) else np.nan
    infl_rows.append(row)

tab9 = pd.DataFrame(infl_rows)
if len(tab9):
    print("=" * 150)
    print(f"TABLE 9c - Inflation from an image-level split ({len(LEAK_SEEDS)} seeds {list(LEAK_SEEDS)}, "
          "identical models and hyperparameters, only the split differs)")
    print("=" * 150)
    show = tab9[["model", "n_seeds", "accuracy_disjoint", "accuracy_leaky", "accuracy_inflation",
                 "macro_f1_disjoint", "macro_f1_leaky", "macro_f1_inflation",
                 "macro_f1_inflation_sd",
                 "macro_f1_leaky_clean", "macro_f1_leaky_contaminated"]]
    print(show.to_string(index=False, float_format=lambda v: f"{v:+.4f}"))
    print("=" * 150)
    save_table(tab9, "table9c_leakage_inflation",
               "Table 9c - Performance inflation attributable to the evaluation protocol")

    # ---- does the protocol change the RANKING, not just the level? ----------
    r_dj = tab9.sort_values("macro_f1_disjoint", ascending=False).model.tolist()
    r_lk = tab9.sort_values("macro_f1_leaky", ascending=False).model.tolist()
    spread = float(tab9.macro_f1_inflation.max() - tab9.macro_f1_inflation.min())
    seed_sd = np.nan
    if "per_run_df" in globals() and isinstance(globals().get("per_run_df"), pd.DataFrame):
        try:
            _pr = globals()["per_run_df"]
            seed_sd = float(_pr.groupby("model")["macro_f1"].std().mean())
        except Exception:  # noqa: BLE001
            pass
    print("\nRANKING BY MACRO-F1")
    print(f"  lesion-disjoint : {' > '.join(r_dj)}")
    print(f"  leakage-prone   : {' > '.join(r_lk)}")
    print(f"  ranking preserved: {r_dj == r_lk}")
    print(f"\n  Inflation spread across architectures (max - min macro-F1): {spread:+.4f}")
    if not np.isnan(seed_sd):
        print(f"  Mean seed-to-seed SD of macro-F1 (Table 3b)                : {seed_sd:.4f}")
        if spread > 2 * seed_sd:
            print("  -> The inflation is NOT uniform across architectures: its spread exceeds")
            print("     twice the seed noise, so the evaluation protocol can reorder conclusions,")
            print("     not merely shift them. This is the finding worth promoting to 3 seeds.")
        else:
            print("  -> The inflation spread is within seed noise: at this budget the protocol")
            print("     shifts the level but there is no evidence it reorders the models.")
            print("     Report as a level effect and do NOT promote to 3 seeds.")
    else:
        print("  (Run Section 10 first to obtain the seed-to-seed SD for the promotion rule.)")

    # ---- Figure 7 ----------------------------------------------------------
    fig, axes = plt.subplots(1, 2, figsize=(13.5, 4.8))
    x = np.arange(len(tab9)); w = 0.36
    axes[0].bar(x - w / 2, tab9.macro_f1_disjoint, w, label="lesion-disjoint (correct)",
                color="#2b6cb0", edgecolor="black", linewidth=0.5)
    axes[0].bar(x + w / 2, tab9.macro_f1_leaky, w, label="image-level random (leaky)",
                color="#c1666b", edgecolor="black", linewidth=0.5)
    for xi, (d, l) in enumerate(zip(tab9.macro_f1_disjoint, tab9.macro_f1_leaky)):
        axes[0].annotate(f"{l - d:+.3f}", (xi, max(d, l) + 0.012), ha="center", fontsize=8)
    axes[0].set_xticks(x)
    axes[0].set_xticklabels(tab9.model, rotation=20, ha="right", fontsize=8)
    axes[0].set_ylabel("macro-F1 (HAM10000 test)")
    axes[0].set_title("Same models, same hyperparameters, different split")
    axes[0].legend(fontsize=8); axes[0].grid(axis="y", alpha=0.25)

    sub = tab9.dropna(subset=["macro_f1_leaky_clean", "macro_f1_leaky_contaminated"])
    if len(sub):
        xs = np.arange(len(sub))
        axes[1].bar(xs - w / 2, sub.macro_f1_leaky_clean, w, label="clean subset",
                    color="#4c9f70", edgecolor="black", linewidth=0.5)
        axes[1].bar(xs + w / 2, sub.macro_f1_leaky_contaminated, w,
                    label="contaminated subset", color="#c1666b", edgecolor="black", linewidth=0.5)
        axes[1].set_xticks(xs)
        axes[1].set_xticklabels(sub.model, rotation=20, ha="right", fontsize=8)
        axes[1].set_ylabel("macro-F1")
        axes[1].set_title("Within the leaky test set: where the inflation comes from")
        axes[1].legend(fontsize=8); axes[1].grid(axis="y", alpha=0.25)
    fig.suptitle("Figure 7 - Effect of the evaluation protocol on reported performance",
                 fontsize=12)
    fig.tight_layout()
    fig.savefig(CFG.fig_dir / "figure7_leakage_ablation.png", dpi=300, bbox_inches="tight")
    plt.close(fig)
    print(f"\nFigure 7 -> {CFG.fig_dir}/figure7_leakage_ablation.png")
else:
    print("Table 9c skipped - the leakage ablation produced no comparable runs.")


---

## 19. Export


In [ ]:
# ============================================================================
# Cell 19.1 - Package everything into a downloadable ZIP (no Google Drive)
# ============================================================================
manifest = {
    "experiment": CFG.experiment_name,
    "generated": time.strftime("%Y-%m-%d %H:%M:%S"),
    "gpu": GPU_NAME,
    "models_evaluated": [MODEL_INFO[k]["display"] for k in AVAILABLE_MODELS],
    "models_excluded": EXCLUDED_MODELS,
    "split_fingerprint": SPLIT_HASH,
    "label_mapping_hash": MAPPING_HASH,
    "external_available": bool(EXT_AVAILABLE),
    "total_gpu_hours_measured": gpu_s / 3600,
    "tables": sorted(p.name for p in CFG.tab_dir.glob("*.csv")),
    "figures": sorted(p.name for p in CFG.fig_dir.glob("*.png")),
}
(CFG.out_dir / "MANIFEST.json").write_text(json.dumps(manifest, indent=2, default=str))

zip_path = Path(CFG.root) / f"{CFG.experiment_name}_results.zip"
with zipfile.ZipFile(zip_path, "w", zipfile.ZIP_DEFLATED) as z:
    for p in CFG.out_dir.rglob("*"):
        if p.is_file():
            z.write(p, p.relative_to(CFG.out_dir.parent))
    for run_dir in CFG.ckpt_dir.iterdir():          # history/config only, not the weights
        if run_dir.is_dir():
            for name in ("history.csv", "config.json"):
                f = run_dir / name
                if f.exists():
                    z.write(f, Path("checkpoints") / run_dir.name / name)

size_mb = zip_path.stat().st_size / 1024**2
print(f"Results archive: {zip_path}  ({size_mb:.1f} MiB)")
print(f"  {len(manifest['tables'])} tables, {len(manifest['figures'])} figures, "
      f"{len(list(CFG.pred_dir.glob('*.npz')))} prediction files")
print("\nModel weights are NOT included (they would add several hundred MiB). To archive them:")
print("  shutil.make_archive('/content/checkpoints_weights', 'zip', '/content/checkpoints')")

try:
    from google.colab import files as colab_files
    colab_files.download(str(zip_path))
except Exception as e:  # noqa: BLE001
    print(f"\nAutomatic download unavailable ({type(e).__name__}). "
          f"Download manually from the Files pane: {zip_path}")

Results archive: /content/mva_dermoscopy_benchmark_v1_results.zip  (12.3 MiB)
  30 tables, 10 figures, 105 prediction files

Model weights are NOT included (they would add several hundred MiB). To archive them:
  shutil.make_archive('/content/checkpoints_weights', 'zip', '/content/checkpoints')


<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>

---
## Appendix — Mapping to the manuscript

| Manuscript element | Produced by | File |
|---|---|---|
| Table 1 — dataset statistics | §4.1, §6.1 | `table1a_*.csv`, `table1b_*.csv`, `table1c_*.csv` |
| Table 2 — training configuration | §8.3 | `table2_training_configuration.csv` |
| Table 3 — HAM10000 test performance | §10.2 | `table3_ham10000_test_performance.csv` |
| Table 4 — external validation (BCN20000) | §11.2 | `table4_external_validation.csv` |
| Table 5 — statistical significance | §12.1 | `table5_statistical_significance.csv` |
| Table 6 — corruption robustness | §13.2 | `table6_robustness_ham10000.csv` |
| Table 7 — computational efficiency | §14.1 | `table7_computational_efficiency.csv` |
| Figure 1 — confusion matrices | §10.3 | `figure1_confusion_matrices.png` |
| Figure 2 — ROC curves | §10.4 | `figure2_roc_curves.png` |
| Figure 3 — performance comparison | §10.5 | `figure3_performance_comparison.png` |
| Figure 4 — corruption degradation | §13.3 | `figure4_corruption_robustness.png` |
| Figure 5 — accuracy vs cost | §14.2 | `figure5_accuracy_vs_cost.png` |
| Reproducibility statement | §16 | `reproducibility.json` |
| Data-availability / leakage statement | §5, §6 | `table_leakage_audit.csv` |

All figures are written at **300 dpi** with tight bounding boxes, which satisfies Springer's
raster-figure requirement for *Machine Vision and Applications*.

**Reporting checklist before submission**

* State the grouping key and the absence of patient IDs in the Methods section.
* Report *all* seeds, including any failed or early-stopped run — `table3b_per_seed_results.csv`
  contains every run and none are hidden.
* Quote both raw and Holm-corrected p-values, as in Table 5.
* Report the measured compute budget from §16, not a nominal figure.
* If any architecture was `EXCLUDED` by the Compatibility Check, say so explicitly and give the
  dependency reason — do not present a three-way comparison as a four-way one.